In [0]:
# ============================================================
# BRONZE SETUP - PROJECT CONFIGURATION
# ============================================================

base_path = "/Volumes/dev_customer360/bronze/landing/olist"

entities = [
    "customers",
    "orders",
    "order_items",
    "payments",
    "reviews",
    "products",
    "sellers",
    "geolocation",
    "category_translation"
]

print("Bronze setup configuration loaded.")
print(f"Base path: {base_path}")
print(f"Entities: {len(entities)}")

Bronze setup configuration loaded.
Base path: /Volumes/dev_customer360/bronze/landing/olist
Entities: 9


In [0]:
# ============================================================
# CREATE ENTITY-SPECIFIC LANDING DIRECTORIES
# ============================================================

for entity in entities:
    dbutils.fs.mkdirs(f"{base_path}/{entity}")

print("Entity directories created successfully.")

Entity directories created successfully.


In [0]:
# ============================================================
# VALIDATE LANDING DIRECTORY STRUCTURE
# ============================================================

display(dbutils.fs.ls(base_path))

path,name,size,modificationTime
dbfs:/Volumes/dev_customer360/bronze/landing/olist/category_translation/,category_translation/,0,1790946405700
dbfs:/Volumes/dev_customer360/bronze/landing/olist/customers/,customers/,0,1790946405701
dbfs:/Volumes/dev_customer360/bronze/landing/olist/geolocation/,geolocation/,0,1790946405701
dbfs:/Volumes/dev_customer360/bronze/landing/olist/initial/,initial/,0,1790946405701
dbfs:/Volumes/dev_customer360/bronze/landing/olist/order_items/,order_items/,0,1790946405701
dbfs:/Volumes/dev_customer360/bronze/landing/olist/orders/,orders/,0,1790946405701
dbfs:/Volumes/dev_customer360/bronze/landing/olist/payments/,payments/,0,1790946405701
dbfs:/Volumes/dev_customer360/bronze/landing/olist/products/,products/,0,1790946405701
dbfs:/Volumes/dev_customer360/bronze/landing/olist/reviews/,reviews/,0,1790946405701
dbfs:/Volumes/dev_customer360/bronze/landing/olist/sellers/,sellers/,0,1790946405702


In [0]:
# ============================================================
# SOURCE FILE MAPPING
# ============================================================

source_base = f"{base_path}/initial"

file_mapping = {
    "olist_customers_dataset.csv": "customers",
    "olist_orders_dataset.csv": "orders",
    "olist_order_items_dataset.csv": "order_items",
    "olist_order_payments_dataset.csv": "payments",
    "olist_order_reviews_dataset.csv": "reviews",
    "olist_products_dataset.csv": "products",
    "olist_sellers_dataset.csv": "sellers",
    "olist_geolocation_dataset.csv": "geolocation",
    "product_category_name_translation.csv": "category_translation"
}

print(f"Source files configured: {len(file_mapping)}")

Source files configured: 9


In [0]:
# ============================================================
# COPY INITIAL SOURCE FILES TO ENTITY DIRECTORIES
# ============================================================

for file_name, entity in file_mapping.items():

    source_path = f"{source_base}/{file_name}"
    target_path = f"{base_path}/{entity}/{file_name}"

    dbutils.fs.cp(
        source_path,
        target_path
    )

    print(f"Copied: {file_name} -> {entity}")

print("\nAll source files copied successfully.")

Copied: olist_customers_dataset.csv -> customers
Copied: olist_orders_dataset.csv -> orders
Copied: olist_order_items_dataset.csv -> order_items
Copied: olist_order_payments_dataset.csv -> payments
Copied: olist_order_reviews_dataset.csv -> reviews
Copied: olist_products_dataset.csv -> products
Copied: olist_sellers_dataset.csv -> sellers
Copied: olist_geolocation_dataset.csv -> geolocation
Copied: product_category_name_translation.csv -> category_translation

All source files copied successfully.


In [0]:
# ============================================================
# VALIDATE ENTITY LANDING FILES
# ============================================================

for entity in entities:

    entity_path = f"{base_path}/{entity}"
    files = dbutils.fs.ls(entity_path)

    print(f"\n{entity.upper()}")

    for file in files:
        print(f"  {file.name}")


CUSTOMERS
  datatype_mismatch_test_01/
  incremental_test_01/
  malformed_test_01.csv
  olist_customers_dataset.csv
  unexpected_schema_test_01/

ORDERS
  olist_orders_dataset.csv

ORDER_ITEMS
  olist_order_items_dataset.csv

PAYMENTS
  olist_order_payments_dataset.csv

REVIEWS
  olist_order_reviews_dataset.csv

PRODUCTS
  olist_products_dataset.csv

SELLERS
  olist_sellers_dataset.csv

GEOLOCATION
  olist_geolocation_dataset.csv

CATEGORY_TRANSLATION
  product_category_name_translation.csv


In [0]:
# ============================================================
# CONFIGURE PROJECT IMPORT PATH
# ============================================================

import os
import sys

PROJECT_ROOT = os.path.abspath("..")

if PROJECT_ROOT not in sys.path:
    sys.path.insert(0, PROJECT_ROOT)

print(f"Project root: {PROJECT_ROOT}")

Project root: /Workspace/Users/karayatprabhakar@gmail.com/customer360


In [0]:
# ============================================================
# IMPORT SOURCE SCHEMA REGISTRY
# ============================================================

from config.schemas import SCHEMA_REGISTRY

print("Schema registry imported successfully.")
print(f"Registered schemas: {len(SCHEMA_REGISTRY)}")

print("\nEntities:")

for entity_name in SCHEMA_REGISTRY:
    print(f"  - {entity_name}")

Schema registry imported successfully.
Registered schemas: 9

Entities:
  - customers
  - orders
  - order_items
  - payments
  - reviews
  - products
  - sellers
  - geolocation
  - category_translation


In [0]:
# ============================================================
# VALIDATE SCHEMA REGISTRY COMPLETENESS
# ============================================================

missing_schemas = [
    entity
    for entity in entities
    if entity not in SCHEMA_REGISTRY
]

if missing_schemas:
    raise ValueError(
        f"Missing schemas for entities: {missing_schemas}"
    )

print("Schema registry validation passed.")
print("All 9 entities have an explicit source schema.")

Schema registry validation passed.
All 9 entities have an explicit source schema.


In [0]:
# ============================================================
# VALIDATE SOURCE FILES AGAINST EXPLICIT SCHEMAS
# ============================================================

for entity in entities:

    entity_path = f"{base_path}/{entity}"
    schema = SCHEMA_REGISTRY[entity]

    df = (
        spark.read
            .format("csv")
            .option("header", "true")
            .option("mode", "PERMISSIVE")
            .schema(schema)
            .load(entity_path)
    )

    print(
        f"{entity:<25} "
        f"rows={df.count():>10,} "
        f"columns={len(df.columns)}"
    )

customers                 rows=    99,442 columns=5
orders                    rows=    99,441 columns=8
order_items               rows=   112,650 columns=7
payments                  rows=   103,886 columns=5
reviews                   rows=   104,162 columns=7
products                  rows=    32,951 columns=9
sellers                   rows=     3,095 columns=4
geolocation               rows= 1,000,163 columns=5
category_translation      rows=        71 columns=2


In [0]:
# ============================================================
# VALIDATE REVIEW SOURCE DATATYPES
# ============================================================

reviews_df = (
    spark.read
        .format("csv")
        .option("header", "true")
        .option("mode", "PERMISSIVE")
        .schema(SCHEMA_REGISTRY["reviews"])
        .load(f"{base_path}/reviews")
)

reviews_df.printSchema()

root
 |-- review_id: string (nullable = true)
 |-- order_id: string (nullable = true)
 |-- review_score: integer (nullable = true)
 |-- review_comment_title: string (nullable = true)
 |-- review_comment_message: string (nullable = true)
 |-- review_creation_date: timestamp (nullable = true)
 |-- review_answer_timestamp: timestamp (nullable = true)



In [0]:
# ============================================================
# REVIEW DATA SAMPLE
# ============================================================

display(
    reviews_df.select(
        "review_id",
        "order_id",
        "review_score",
        "review_creation_date",
        "review_answer_timestamp"
    ).limit(20)
)

review_id,order_id,review_score,review_creation_date,review_answer_timestamp
7bc2406110b926393aa56f80a40eba40,73fc7af87114b39712e6da79b0a377eb,4,2018-01-18T00:00:00.000Z,2018-01-18T21:46:59.000Z
80e641a11e56f04c1ad469d5645fdfde,a548910a1c6147796b98fdf73dbeba33,5,2018-03-10T00:00:00.000Z,2018-03-11T03:05:13.000Z
228ce5500dc1d8e020d8d1322874b6f0,f9e4b658b201a9f2ecdecbb34bed034b,5,2018-02-17T00:00:00.000Z,2018-02-18T14:36:24.000Z
e64fb393e7b32834bb789ff8bb30750e,658677c97b385a9be170737859d3511b,5,2017-04-21T00:00:00.000Z,2017-04-21T22:02:06.000Z
f7c4243c7fe1938f181bec41a392bdeb,8e6bfb81e283fa7e4f11123a3fb894f1,5,2018-03-01T00:00:00.000Z,2018-03-02T10:26:53.000Z
15197aa66ff4d0650b5434f1b46cda19,b18dcdf73be66366873cd26c5724d1dc,1,2018-04-13T00:00:00.000Z,2018-04-16T00:39:37.000Z
07f9bee5d1b850860defd761afa7ff16,e48aa0d2dcec3a2e87348811bcfdf22b,5,2017-07-16T00:00:00.000Z,2017-07-18T19:30:34.000Z
7c6400515c67679fbee952a7525281ef,c31a859e34e3adac22f376954e19b39d,5,2018-08-14T00:00:00.000Z,2018-08-14T21:36:06.000Z
a3f6f7f6f433de0aefbb97da197c554c,9c214ac970e84273583ab523dfafd09b,5,2017-05-17T00:00:00.000Z,2017-05-18T12:05:37.000Z
8670d52e15e00043ae7de4c01cc2fe06,b9bf720beb4ab3728760088589c62129,4,2018-05-22T00:00:00.000Z,2018-05-23T16:45:47.000Z


In [0]:
from config.ingestion_config import INGESTION_CONFIGS

customer_config = INGESTION_CONFIGS["customers"]

print("Entity:", customer_config.entity_name)
print("Source system:", customer_config.source_system)
print("Source path:", customer_config.source_path)
print("Target table:", customer_config.target_table)
print("File format:", customer_config.file_format)
print("Business columns:", customer_config.business_columns)

Entity: customers
Source system: olist
Source path: /Volumes/dev_customer360/bronze/landing/olist/customers
Target table: bronze_cutomers
File format: csv
Business columns: ('customer_id', 'customer_unique_id', 'customer_zip_code_prefix', 'customer_city', 'customer_state')


In [0]:
print("CUSTOMERS SCHEMA")
print("=" * 60)

for field in customer_config.schema.fields:
    print(
        f"{field.name:<35} "
        f"{field.dataType.simpleString():<12} "
        f"nullable={field.nullable}"
    )

CUSTOMERS SCHEMA
customer_id                         string       nullable=True
customer_unique_id                  string       nullable=True
customer_zip_code_prefix            int          nullable=True
customer_city                       string       nullable=True
customer_state                      string       nullable=True


In [0]:
from framework.auto_loader_reader import AutoLoaderReader
from config.ingestion_config import INGESTION_CONFIGS


customer_config = INGESTION_CONFIGS["customers"]

reader = AutoLoaderReader(spark)

customers_stream_df = reader.read(customer_config)

In [0]:
print(
    "Is streaming DataFrame:",
    customers_stream_df.isStreaming
)

Is streaming DataFrame: True


In [0]:
customers_stream_df.printSchema()

root
 |-- customer_id: string (nullable = true)
 |-- customer_unique_id: string (nullable = true)
 |-- customer_zip_code_prefix: integer (nullable = true)
 |-- customer_city: string (nullable = true)
 |-- customer_state: string (nullable = true)
 |-- _rescued_data: string (nullable = true)



In [0]:
from framework.metadata_enricher import MetadataEnricher


metadata_enricher = MetadataEnricher()

customers_enriched_df = metadata_enricher.enrich(
    customers_stream_df,
    customer_config
)

In [0]:
print(
    "Is enriched DataFrame streaming:",
    customers_enriched_df.isStreaming
)

Is enriched DataFrame streaming: True


In [0]:
customers_enriched_df.printSchema()

root
 |-- customer_id: string (nullable = true)
 |-- customer_unique_id: string (nullable = true)
 |-- customer_zip_code_prefix: integer (nullable = true)
 |-- customer_city: string (nullable = true)
 |-- customer_state: string (nullable = true)
 |-- _rescued_data: string (nullable = true)
 |-- _source_system: string (nullable = false)
 |-- _source_entity: string (nullable = false)
 |-- _source_file_path: string (nullable = false)
 |-- _source_file_name: string (nullable = false)
 |-- _source_file_size: long (nullable = false)
 |-- _source_file_modification_time: timestamp (nullable = false)
 |-- _ingestion_timestamp: timestamp (nullable = false)
 |-- _ingestion_date: date (nullable = false)



In [0]:
from framework.record_hasher import RecordHasher


record_hasher = RecordHasher()

customers_final_df = record_hasher.add_hash(
    customers_enriched_df,
    customer_config
)

In [0]:
print(
    "Is final DataFrame streaming:",
    customers_final_df.isStreaming
)

Is final DataFrame streaming: True


In [0]:
customers_final_df.printSchema()

root
 |-- customer_id: string (nullable = true)
 |-- customer_unique_id: string (nullable = true)
 |-- customer_zip_code_prefix: integer (nullable = true)
 |-- customer_city: string (nullable = true)
 |-- customer_state: string (nullable = true)
 |-- _rescued_data: string (nullable = true)
 |-- _source_system: string (nullable = false)
 |-- _source_entity: string (nullable = false)
 |-- _source_file_path: string (nullable = false)
 |-- _source_file_name: string (nullable = false)
 |-- _source_file_size: long (nullable = false)
 |-- _source_file_modification_time: timestamp (nullable = false)
 |-- _ingestion_timestamp: timestamp (nullable = false)
 |-- _ingestion_date: date (nullable = false)
 |-- _record_hash: string (nullable = true)



In [0]:
import importlib
import config.ingestion_config

importlib.reload(config.ingestion_config)

INGESTION_CONFIGS = config.ingestion_config.INGESTION_CONFIGS

In [0]:
print("Total configurations:", len(INGESTION_CONFIGS))

for entity_name, config in INGESTION_CONFIGS.items():
    print(
        f"{entity_name:<25}"
        f"target={config.target_table:<30}"
        f"columns={len(config.business_columns):<3}"
        f"path={config.source_path}"
    )

Total configurations: 9
customers                target=bronze_customers              columns=5  path=/Volumes/dev_customer360/bronze/landing/olist/customers
orders                   target=bronze_orders                 columns=8  path=/Volumes/dev_customer360/bronze/landing/olist/orders
order_items              target=bronze_order_items            columns=7  path=/Volumes/dev_customer360/bronze/landing/olist/order_items
payments                 target=bronze_payments               columns=5  path=/Volumes/dev_customer360/bronze/landing/olist/payments
reviews                  target=bronze_reviews                columns=7  path=/Volumes/dev_customer360/bronze/landing/olist/reviews
products                 target=bronze_products               columns=9  path=/Volumes/dev_customer360/bronze/landing/olist/products
sellers                  target=bronze_sellers                columns=4  path=/Volumes/dev_customer360/bronze/landing/olist/sellers
geolocation              target=bronze_geoloc

In [0]:
for entity_name, config in INGESTION_CONFIGS.items():

    schema_columns = {
        field.name
        for field in config.schema.fields
    }

    missing_columns = (
        set(config.business_columns)
        - schema_columns
    )

    if missing_columns:
        print(f"❌ {entity_name}: missing {missing_columns}")
    else:
        print(f"✅ {entity_name}: configuration valid")

✅ customers: configuration valid
✅ orders: configuration valid
✅ order_items: configuration valid
✅ payments: configuration valid
✅ reviews: configuration valid
✅ products: configuration valid
✅ sellers: configuration valid
✅ geolocation: configuration valid
✅ category_translation: configuration valid


In [0]:
reviews_path = (
    "/Volumes/dev_customer360/bronze/landing/"
    "olist/reviews/olist_order_reviews_dataset.csv"
)

raw_reviews = spark.read.text(reviews_path)

display(
    raw_reviews.filter(
        raw_reviews.value.contains(
            "a0a3535ba5de64434f49701505c48592"
        )
    )
)

value
"""a0a3535ba5de64434f49701505c48592"",""8564eda5247ce8353cdf36e0ccd2f2c7"",1,,""JÁ SOU CLIENTE DA AMERICAS FAZ TEMPO, NUNCA TIVE PROBLEMAS. PORÉM, ESTA LOJA """"targaryen"""", FOI A MINHA PRIMEIRA COMPRA E NÃO RECOMENDO, POIS NÃO CUMPREM PARA DE ENTREGA ESTABELECIDO."


In [0]:
from config.schemas import SCHEMA_REGISTRY

reviews_test_df = (
    spark.read
        .format("csv")
        .option("header", "true")
        .option("quote", '"')
        .option("escape", '"')
        .option("multiLine", "true")
        .schema(SCHEMA_REGISTRY["reviews"])
        .load(reviews_path)
)

In [0]:
display(
    reviews_test_df.filter(
        "review_id = 'a0a3535ba5de64434f49701505c48592'"
    )
)

review_id,order_id,review_score,review_comment_title,review_comment_message,review_creation_date,review_answer_timestamp
a0a3535ba5de64434f49701505c48592,8564eda5247ce8353cdf36e0ccd2f2c7,1,null,"JÁ SOU CLIENTE DA AMERICAS FAZ TEMPO, NUNCA TIVE PROBLEMAS. PORÉM, ESTA LOJA ""targaryen"", FOI A MINHA PRIMEIRA COMPRA E NÃO RECOMENDO, POIS NÃO CUMPREM PARA DE ENTREGA ESTABELECIDO.",2018-04-21T00:00:00.000Z,2018-04-23T16:00:24.000Z


In [0]:
print("Row count:", reviews_test_df.count())

Row count: 99224


In [0]:
reviews_test_df_2 = (
    spark.read
        .format("csv")
        .option("header", "true")
        .option("quote", '"')
        .option("escape", '"')
        .schema(SCHEMA_REGISTRY["reviews"])
        .load(reviews_path)
)

print("Row count:", reviews_test_df_2.count())

Row count: 104162


In [0]:
display(
    reviews_test_df_2.filter(
        "review_id = 'a0a3535ba5de64434f49701505c48592'"
    )
)

review_id,order_id,review_score,review_comment_title,review_comment_message,review_creation_date,review_answer_timestamp
a0a3535ba5de64434f49701505c48592,8564eda5247ce8353cdf36e0ccd2f2c7,1,null,"JÁ SOU CLIENTE DA AMERICAS FAZ TEMPO, NUNCA TIVE PROBLEMAS. PORÉM, ESTA LOJA ""targaryen"", FOI A MINHA PRIMEIRA COMPRA E NÃO RECOMENDO, POIS NÃO CUMPREM PARA DE ENTREGA ESTABELECIDO.",null,null


In [0]:
from pyspark.sql.functions import col

print(
    "Null review IDs:",
    reviews_test_df_2.filter(
        col("review_id").isNull()
    ).count()
)

Null review IDs: 1


In [0]:
display(
    reviews_test_df_2
        .filter(col("review_id").isNull())
)

review_id,order_id,review_score,review_comment_title,review_comment_message,review_creation_date,review_answer_timestamp
null,material de boa qualidade.Agora é amarelo mesmo,null,"mas e muito bonito.eu recomendo""",2018-01-06 00:00:00,2018-01-08T14:20:31.000Z,null


In [0]:
print(
    "Null creation dates:",
    reviews_test_df_2
        .filter(col("review_creation_date").isNull())
        .count()
)

print(
    "Null answer timestamps:",
    reviews_test_df_2
        .filter(col("review_answer_timestamp").isNull())
        .count()
)

Null creation dates: 8767
Null answer timestamps: 8785


In [0]:
from pyspark.sql.functions import col

print("Total rows:", reviews_test_df.count())

print(
    "Valid review IDs:",
    reviews_test_df.filter(
        col("review_id").rlike("^[0-9a-f]{32}$")
    ).count()
)

print(
    "Invalid review IDs:",
    reviews_test_df.filter(
        col("review_id").isNotNull()
        & ~col("review_id").rlike("^[0-9a-f]{32}$")
    ).count()
)

print(
    "Null review IDs:",
    reviews_test_df.filter(
        col("review_id").isNull()
    ).count()
)

Total rows: 99224
Valid review IDs: 99224
Invalid review IDs: 0
Null review IDs: 0


In [0]:
import os
import sys

PROJECT_ROOT = os.path.abspath("..")

if PROJECT_ROOT not in sys.path:
    sys.path.insert(0, PROJECT_ROOT)

print(f"Project root: {PROJECT_ROOT}")

from config.quality_rules import QUALITY_RULE_REGISTRY

Project root: /Workspace/Users/karayatprabhakar@gmail.com/customer360


In [0]:
customer_rules = QUALITY_RULE_REGISTRY["customers"]

print("Number of customer DQ rules:", len(customer_rules))

for rule in customer_rules:
    print(rule.rule_name, "|", rule.action, "|", rule.condition)

Number of customer DQ rules: 6
CUSTOMER_ID_NOT_NULL | QUARANTINE | customer_id IS NOT NULL
CUSTOMER_UNIQUE_ID_NOT_NULL | QUARANTINE | customer_unique_id IS NOT NULL
CUSTOMER_ZIP_NOT_NULL | QUARANTINE | customer_zip_code_prefix IS NOT NULL
CUSTOMER_CITY_NOT_BLANK | QUARANTINE | customer_city IS NOT NULL AND TRIM(customer_city) <> ''
CUSTOMER_STATE_VALID | QUARANTINE | customer_state IS NOT NULL AND customer_state RLIKE '^[A-Z]{2}$'
CUSTOMER_NOT_RESCUED | QUARANTINE | _rescued_data IS NULL


In [0]:
from config.quality_rules import QUALITY_RULE_REGISTRY
from framework.quality_validator import QualityValidator

In [0]:
# Read the existing Bronze table as a batch DataFrame for testing
customers_df = spark.table("dev_customer360.bronze.bronze_customers")

# Get configured Customer DQ riles
customer_rules = QUALITY_RULE_REGISTRY["customers"]

# Create validator
validator = QualityValidator()

# Apply DQ Rules
validated_customers_df = validator.apply_rules(customers_df, customer_rules)

In [0]:
display(
    validated_customers_df.select(
        "customer_id",
        "customer_unique_id",
        "customer_zip_code_prefix",
        "customer_city",
        "customer_state",
        "_rescued_data",
        "_dq_failed_rules"
    ).filter("customer_id LIKE 'TEST_%'")
)

customer_id,customer_unique_id,customer_zip_code_prefix,customer_city,customer_state,_rescued_data,_dq_failed_rules
TEST_CUST_BAD_TYPE_001,TEST_UNIQUE_BAD_TYPE_001,null,test_bad_type_city,TS,"{""customer_zip_code_prefix"":""NOT_A_NUMBER"",""_file_path"":""/Volumes/dev_customer360/bronze/landing/olist/customers/datatype_mismatch_test_01/part-00000-tid-8643935039769840623-5f45d360-9fdd-4df1-bca5-9f59004f3768-128-1-c000.csv""}","List(CUSTOMER_ZIP_NOT_NULL, CUSTOMER_NOT_RESCUED)"
TEST_CUST_SCHEMA_001,TEST_UNIQUE_SCHEMA_001,110003,schema_test_city,TS,"{""customer_loyalty_tier"":""GOLD"",""_file_path"":""/Volumes/dev_customer360/bronze/landing/olist/customers/unexpected_schema_test_01/part-00000-tid-8962362420997821543-52f63cd8-86a4-419d-9b0a-e72754037d6a-133-1-c000.csv""}",List(CUSTOMER_NOT_RESCUED)
TEST_CUST_001,TEST_UNIQUE_001,110001,test_city_1,TS,null,List()
TEST_CUST_002,TEST_UNIQUE_002,110002,test_city_2,TS,null,List()
TEST_CORRUPT_001,TEST_UNIQUE_CORRUPT_001,110004,"broken city,TS",null,null,List(CUSTOMER_STATE_VALID)


In [0]:
# Read the existing Bronze table as a batch DataFrame for testing
customers_df = spark.table("dev_customer360.bronze.bronze_customers")

# Create validator
validator = QualityValidator()

# Apply DQ Rules
validated_customers_df = validator.apply_rules(customers_df, QUALITY_RULE_REGISTRY["customers"])

display(
    validated_customers_df\
        .filter("customer_id LIKE 'TEST_%'")
        .select(
            "customer_id",
            "customer_zip_code_prefix",
            "customer_state",
            "_dq_status",
            "_dq_failed_rules",
            "_dq_checked_at"
        )
)

customer_id,customer_zip_code_prefix,customer_state,_dq_status,_dq_failed_rules,_dq_checked_at
TEST_CUST_BAD_TYPE_001,null,TS,QUARANTINED,"List(CUSTOMER_ZIP_NOT_NULL, CUSTOMER_NOT_RESCUED)",2026-10-03T10:04:32.396Z
TEST_CUST_SCHEMA_001,110003,TS,QUARANTINED,List(CUSTOMER_NOT_RESCUED),2026-10-03T10:04:32.396Z
TEST_CUST_001,110001,TS,VALID,List(),2026-10-03T10:04:32.396Z
TEST_CUST_002,110002,TS,VALID,List(),2026-10-03T10:04:32.396Z
TEST_CORRUPT_001,110004,null,QUARANTINED,List(CUSTOMER_STATE_VALID),2026-10-03T10:04:32.396Z


In [0]:
validated_customers_df.groupBy(
    "_dq_status"
).count().orderBy(
    "_dq_status"
).show()

+-----------+-----+
| _dq_status|count|
+-----------+-----+
|QUARANTINED|    3|
|      VALID|99443|
+-----------+-----+



In [0]:
print("Bronze customers:", customers_df.count())

print(
    "Validated customers:",
    validated_customers_df.count()
)

Bronze customers: 99446
Validated customers: 99446


In [0]:
valid_customers_df = validator.get_valid_records(validated_customers_df)
quarantined_customers_df = validator.get_quarantined_records(validated_customers_df)

print("Valid customers:", valid_customers_df.count())
print("Quarantined customers:", quarantined_customers_df.count())
print("Reconciled:", customers_df.count() == valid_customers_df.count() + quarantined_customers_df.count())

Valid customers: 99443
Quarantined customers: 3
Reconciled: True


In [0]:
%sql
SELECT
    COUNT(*) AS validated_count
FROM dev_customer360.silver.validated_customers;

validated_count
99443


In [0]:
%sql
SELECT
    COUNT(*) AS quarantine_count
FROM dev_customer360.ops.quarantine_customers;

quarantine_count
3


In [0]:
%sql
SELECT
    customer_id,
    customer_zip_code_prefix,
    customer_state,
    _dq_status,
    _dq_failed_rules,
    _rescued_data,
    _source_file_name,
    _dq_checked_at
FROM dev_customer360.ops.quarantine_customers
ORDER BY customer_id;

customer_id,customer_zip_code_prefix,customer_state,_dq_status,_dq_failed_rules,_rescued_data,_source_file_name,_dq_checked_at
TEST_CORRUPT_001,110004,null,QUARANTINED,List(CUSTOMER_STATE_VALID),null,malformed_test_01.csv,2026-10-03T10:42:18.044Z
TEST_CUST_BAD_TYPE_001,null,TS,QUARANTINED,"List(CUSTOMER_ZIP_NOT_NULL, CUSTOMER_NOT_RESCUED)","{""customer_zip_code_prefix"":""NOT_A_NUMBER"",""_file_path"":""/Volumes/dev_customer360/bronze/landing/olist/customers/datatype_mismatch_test_01/part-00000-tid-8643935039769840623-5f45d360-9fdd-4df1-bca5-9f59004f3768-128-1-c000.csv""}",part-00000-tid-8643935039769840623-5f45d360-9fdd-4df1-bca5-9f59004f3768-128-1-c000.csv,2026-10-03T10:42:18.044Z
TEST_CUST_SCHEMA_001,110003,TS,QUARANTINED,List(CUSTOMER_NOT_RESCUED),"{""customer_loyalty_tier"":""GOLD"",""_file_path"":""/Volumes/dev_customer360/bronze/landing/olist/customers/unexpected_schema_test_01/part-00000-tid-8962362420997821543-52f63cd8-86a4-419d-9b0a-e72754037d6a-133-1-c000.csv""}",part-00000-tid-8962362420997821543-52f63cd8-86a4-419d-9b0a-e72754037d6a-133-1-c000.csv,2026-10-03T10:42:18.044Z


In [0]:
%sql
SELECT
    COUNT(*) AS total_rows,

    -- Key checks
    COUNT_IF(order_id IS NULL) AS null_order_id,
    COUNT_IF(customer_id IS NULL) AS null_customer_id,

    -- Status checks
    COUNT_IF(
        order_status IS NULL
        OR TRIM(order_status) = ''
    ) AS null_or_blank_status,

    -- Core purchase timestamp
    COUNT_IF(
        order_purchase_timestamp IS NULL
    ) AS null_purchase_timestamp,

    -- Delivery expectation
    COUNT_IF(
        order_estimated_delivery_date IS NULL
    ) AS null_estimated_delivery_date,

    -- Timestamp sequence checks
    COUNT_IF(
        order_approved_at IS NOT NULL
        AND order_approved_at < order_purchase_timestamp
    ) AS approval_before_purchase,

    COUNT_IF(
        order_delivered_carrier_date IS NOT NULL
        AND order_approved_at IS NOT NULL
        AND order_delivered_carrier_date < order_approved_at
    ) AS carrier_before_approval,

    COUNT_IF(
        order_delivered_customer_date IS NOT NULL
        AND order_delivered_carrier_date IS NOT NULL
        AND order_delivered_customer_date < order_delivered_carrier_date
    ) AS customer_delivery_before_carrier,

    -- Parsing/schema problems
    COUNT_IF(
        _rescued_data IS NOT NULL
    ) AS rescued_records

FROM dev_customer360.bronze.bronze_orders;

total_rows,null_order_id,null_customer_id,null_or_blank_status,null_purchase_timestamp,null_estimated_delivery_date,approval_before_purchase,carrier_before_approval,customer_delivery_before_carrier,rescued_records
99441,0,0,0,0,0,0,1359,23,0


In [0]:
%sql
SELECT
    order_status,
    COUNT(*) AS row_count
FROM dev_customer360.bronze.bronze_orders
GROUP BY order_status
ORDER BY row_count DESC;

order_status,row_count
delivered,96478
shipped,1107
canceled,625
unavailable,609
invoiced,314
processing,301
created,5
approved,2


In [0]:
%sql
SELECT
    order_status,
    COUNT(*) AS affected_rows
FROM dev_customer360.bronze.bronze_orders
WHERE
    order_delivered_carrier_date IS NOT NULL
    AND order_approved_at IS NOT NULL
    AND order_delivered_carrier_date < order_approved_at
GROUP BY order_status
ORDER BY affected_rows DESC;

order_status,affected_rows
delivered,1350
shipped,9


In [0]:
%sql
SELECT
    order_id,
    order_status,
    order_purchase_timestamp,
    order_approved_at,
    order_delivered_carrier_date,
    order_delivered_customer_date,
    order_estimated_delivery_date,
    TIMESTAMPDIFF(
        MINUTE,
        order_delivered_carrier_date,
        order_approved_at
    ) AS carrier_before_approval_minutes

FROM dev_customer360.bronze.bronze_orders
WHERE
    order_delivered_carrier_date IS NOT NULL
    AND order_approved_at IS NOT NULL
    AND order_delivered_carrier_date < order_approved_at

ORDER BY carrier_before_approval_minutes DESC

LIMIT 20;

order_id,order_status,order_purchase_timestamp,order_approved_at,order_delivered_carrier_date,order_delivered_customer_date,order_estimated_delivery_date,carrier_before_approval_minutes
7c48bb55e8e4f7e56d412e9653db37bc,delivered,2018-07-16T18:40:53.000Z,2018-07-16T18:50:22.000Z,2018-01-26T13:35:00.000Z,2018-07-23T20:04:45.000Z,2018-08-07T00:00:00.000Z,246555
1fab4ac9d85079b3da72a11475ae1685,delivered,2017-09-01T19:04:22.000Z,2017-09-13T22:06:11.000Z,2017-09-04T13:10:23.000Z,2017-09-08T20:13:03.000Z,2017-09-20T00:00:00.000Z,13495
0184d4ddb259e1a4cfc2871888cf97b8,delivered,2017-09-01T20:04:28.000Z,2017-09-13T22:17:15.000Z,2017-09-04T14:05:50.000Z,2017-09-09T15:12:44.000Z,2017-09-20T00:00:00.000Z,13451
1378f9601350615613cc8832d6789c5d,delivered,2017-09-01T20:28:02.000Z,2017-09-13T22:03:51.000Z,2017-09-04T18:07:55.000Z,2017-09-13T22:24:46.000Z,2017-09-29T00:00:00.000Z,13195
8554cb37f7158cb0b082a841d24a4589,delivered,2017-09-01T18:40:44.000Z,2017-09-13T21:58:04.000Z,2017-09-04T19:12:19.000Z,2017-09-08T20:07:45.000Z,2017-10-02T00:00:00.000Z,13125
cf72398d0690f841271b695bbfda82d2,delivered,2017-09-01T18:45:33.000Z,2017-09-13T22:04:39.000Z,2017-09-04T20:12:41.000Z,2017-09-11T14:15:02.000Z,2017-09-21T00:00:00.000Z,13071
40de47dfa620d667117e4a6067b6e1ec,delivered,2017-09-01T20:05:55.000Z,2017-09-13T21:58:38.000Z,2017-09-04T20:36:58.000Z,2017-09-08T20:41:16.000Z,2017-09-22T00:00:00.000Z,13041
bc4854efd86d9f42140c951c595d20c1,delivered,2017-09-01T20:05:42.000Z,2017-09-13T22:00:51.000Z,2017-09-04T20:49:57.000Z,2017-09-06T22:15:45.000Z,2017-09-20T00:00:00.000Z,13030
77ca435b03fbf991e5027e3776e37885,delivered,2017-09-01T18:49:54.000Z,2017-09-13T21:56:08.000Z,2017-09-04T20:50:00.000Z,2017-09-30T17:33:43.000Z,2017-09-26T00:00:00.000Z,13026
580f3268bc2075c5961b2d2929c7a35b,delivered,2017-09-01T20:17:09.000Z,2017-09-13T22:03:42.000Z,2017-09-05T11:58:18.000Z,2017-09-18T17:52:20.000Z,2017-09-25T00:00:00.000Z,12125


In [0]:
%sql
SELECT
    COUNT(*) AS orphan_order_rows,
    COUNT(DISTINCT o.customer_id) AS orphan_customer_ids
FROM dev_customer360.bronze.bronze_orders o
LEFT ANTI JOIN dev_customer360.bronze.bronze_customers c
    ON o.customer_id = c.customer_id;

orphan_order_rows,orphan_customer_ids
0,0


In [0]:
from config.quality_rules import QUALITY_RULE_REGISTRY
from framework.quality_validator import QualityValidator

customer_df = spark.table(
    "dev_customer360.bronze.bronze_customers"
)

validator = QualityValidator()

validated_df = validator.apply_rules(
    customer_df,
    QUALITY_RULE_REGISTRY["customers"]
)

validated_df.groupBy("_dq_status").count().show()

+-----------+-----+
| _dq_status|count|
+-----------+-----+
|      VALID|99443|
|QUARANTINED|    3|
+-----------+-----+



In [0]:
valid_count = validator.get_valid_records(validated_df).count()
quarantine_count = validator.get_quarantined_records(validated_df).count()
total_count = validated_df.count()

print(f"Total customers: {total_count}")
print(f"Eligible customers: {valid_count}")
print(f"Quarantined customers: {quarantine_count}")
print(f"Reconciled: {valid_count + quarantine_count == total_count}")

Total customers: 99446
Eligible customers: 99443
Quarantined customers: 3
Reconciled: True


In [0]:
import os
import sys

PROJECT_ROOT = os.path.abspath("..")

if PROJECT_ROOT not in sys.path:
    sys.path.insert(0, PROJECT_ROOT)

print(f"Project root: {PROJECT_ROOT}")

Project root: /Workspace/Users/karayatprabhakar@gmail.com/customer360


In [0]:
from config.quality_rules import QUALITY_RULE_REGISTRY
from framework.quality_validator import QualityValidator

orders_df = spark.table(
    "dev_customer360.bronze.bronze_orders"
)

validator = QualityValidator()

validated_orders_df = validator.apply_rules(
    orders_df,
    QUALITY_RULE_REGISTRY["orders"]
)

validated_orders_df.groupBy("_dq_status").count().show()

+----------+-----+
|_dq_status|count|
+----------+-----+
|     VALID|98059|
|   WARNING| 1382|
+----------+-----+



In [0]:
from pyspark.sql.functions import explode, col

(
    validated_orders_df
        .select(
            "order_id",
            "_dq_status",
            explode("_dq_failed_rules").alias("failed_rule")
        )
        .groupBy("failed_rule", "_dq_status")
        .count()
        .orderBy("failed_rule")
        .show(truncate=False)
)

+---------------------------------+----------+-----+
|failed_rule                      |_dq_status|count|
+---------------------------------+----------+-----+
|ORDER_CARRIER_NOT_BEFORE_APPROVAL|WARNING   |1359 |
|ORDER_DELIVERY_NOT_BEFORE_CARRIER|WARNING   |23   |
+---------------------------------+----------+-----+



In [0]:
%sql
SELECT
    _dq_status,
    COUNT(*) AS row_count
FROM dev_customer360.silver.validated_orders
GROUP BY _dq_status
ORDER BY _dq_status;

_dq_status,row_count
VALID,98059
WARNING,1382


In [0]:
%sql
SELECT
    (SELECT COUNT(*) FROM dev_customer360.bronze.bronze_orders) AS bronze_count,
    (SELECT COUNT(*) FROM dev_customer360.silver.validated_orders) AS eligible_count,
    (SELECT COUNT(*) FROM dev_customer360.ops.quarantine_orders) AS quarantine_count;

bronze_count,eligible_count,quarantine_count
99441,99441,0


In [0]:
%sql
SELECT
    COUNT(*) AS total_rows,
    COUNT_IF(order_id IS NULL) AS null_order_id,
    COUNT_IF(order_item_id IS NULL) AS null_order_item_id,
    COUNT_IF(product_id IS NULL) AS null_product_id,
    COUNT_IF(seller_id IS NULL) AS null_seller_id,
    COUNT_IF(shipping_limit_date IS NULL) AS null_shipping_limit_date,
    COUNT_IF(price IS NULL) AS null_price,
    COUNT_IF(price <= 0) AS non_positive_price,
    COUNT_IF(freight_value IS NULL) AS null_freight_value,
    COUNT_IF(freight_value < 0) AS negative_freight,
    COUNT_IF(_rescued_data IS NOT NULL) AS rescued_records
FROM dev_customer360.bronze.bronze_order_items;

total_rows,null_order_id,null_order_item_id,null_product_id,null_seller_id,null_shipping_limit_date,null_price,non_positive_price,null_freight_value,negative_freight,rescued_records
112650,0,0,0,0,0,0,0,0,0,0


In [0]:
%sql
SELECT
    COUNT(*) AS duplicate_key_groups,
    COALESCE(SUM(row_count - 1), 0) AS duplicate_rows
FROM (
    SELECT
        order_id,
        order_item_id,
        COUNT(*) AS row_count
    FROM dev_customer360.bronze.bronze_order_items
    GROUP BY
        order_id,
        order_item_id
    HAVING COUNT(*) > 1
);

duplicate_key_groups,duplicate_rows
0,0


In [0]:
%sql
-- 1. Order Items whose Order does not exist
SELECT COUNT(*) AS orphan_order_items
FROM dev_customer360.bronze.bronze_order_items oi
LEFT ANTI JOIN dev_customer360.bronze.bronze_orders o
    ON oi.order_id = o.order_id;

orphan_order_items
0


In [0]:
%sql
-- 2. Order Items whose Product does not exist
SELECT COUNT(*) AS orphan_product_items
FROM dev_customer360.bronze.bronze_order_items oi
LEFT ANTI JOIN dev_customer360.bronze.bronze_products p
    ON oi.product_id = p.product_id;

orphan_product_items
0


In [0]:
%sql
-- 3. Order Items whose Seller does not exist
SELECT COUNT(*) AS orphan_seller_items
FROM dev_customer360.bronze.bronze_order_items oi
LEFT ANTI JOIN dev_customer360.bronze.bronze_sellers s
    ON oi.seller_id = s.seller_id;

orphan_seller_items
0


In [0]:
from config.quality_rules import QUALITY_RULE_REGISTRY
from framework.quality_validator import QualityValidator

order_items_df = spark.table(
    "dev_customer360.bronze.bronze_order_items"
)

validator = QualityValidator()

validated_order_items_df = validator.apply_rules(
    order_items_df,
    QUALITY_RULE_REGISTRY["order_items"]
)

validated_order_items_df.groupBy(
    "_dq_status"
).count().show()

+----------+------+
|_dq_status| count|
+----------+------+
|     VALID|112650|
+----------+------+



In [0]:
%sql
SELECT
    _dq_status,
    COUNT(*) AS row_count
FROM dev_customer360.silver.validated_order_items
GROUP BY _dq_status;

_dq_status,row_count
VALID,112650


In [0]:
%sql
SELECT
    (SELECT COUNT(*) FROM dev_customer360.bronze.bronze_order_items) AS bronze_count,
    (SELECT COUNT(*) FROM dev_customer360.silver.validated_order_items) AS eligible_count,
    (SELECT COUNT(*) FROM dev_customer360.ops.quarantine_order_items) AS quarantine_count;

bronze_count,eligible_count,quarantine_count
112650,112650,0


In [0]:
%sql
SELECT
    COUNT(*) AS total_rows,

    COUNT_IF(order_id IS NULL) AS null_order_id,
    COUNT_IF(payment_sequential IS NULL) AS null_payment_sequential,

    COUNT_IF(payment_type IS NULL OR TRIM(payment_type) = '')
        AS null_or_blank_payment_type,

    COUNT_IF(payment_installments IS NULL)
        AS null_installments,

    COUNT_IF(payment_installments < 0)
        AS negative_installments,

    COUNT_IF(payment_value IS NULL)
        AS null_payment_value,

    COUNT_IF(payment_value < 0)
        AS negative_payment_value,

    COUNT_IF(_rescued_data IS NOT NULL)
        AS rescued_records

FROM dev_customer360.bronze.bronze_payments;

total_rows,null_order_id,null_payment_sequential,null_or_blank_payment_type,null_installments,negative_installments,null_payment_value,negative_payment_value,rescued_records
103886,0,0,0,0,0,0,0,0


In [0]:
%sql
SELECT
    payment_type,
    COUNT(*) AS row_count,
    MIN(payment_installments) AS min_installments,
    MAX(payment_installments) AS max_installments,
    COUNT_IF(payment_installments = 0) AS zero_installment_rows,
    MIN(payment_value) AS min_payment_value,
    MAX(payment_value) AS max_payment_value,
    COUNT_IF(payment_value = 0) AS zero_payment_value_rows
FROM dev_customer360.bronze.bronze_payments
GROUP BY payment_type
ORDER BY row_count DESC;

payment_type,row_count,min_installments,max_installments,zero_installment_rows,min_payment_value,max_payment_value,zero_payment_value_rows
credit_card,76795,0,24,2,0.01,13664.08,0
boleto,19784,1,1,0,11.62,7274.88,0
voucher,5775,1,1,0,0.0,3184.34,6
debit_card,1529,1,1,0,13.38,4445.5,0
not_defined,3,1,1,0,0.0,0.0,3


In [0]:
%sql
SELECT
    COUNT(*) AS duplicate_key_groups,
    COALESCE(SUM(row_count - 1), 0) AS duplicate_rows
FROM (
    SELECT
        order_id,
        payment_sequential,
        COUNT(*) AS row_count
    FROM dev_customer360.bronze.bronze_payments
    GROUP BY
        order_id,
        payment_sequential
    HAVING COUNT(*) > 1
);

duplicate_key_groups,duplicate_rows
0,0


In [0]:
%sql
Select * from dev_customer360.bronze.bronze_payments

order_id,payment_sequential,payment_type,payment_installments,payment_value,_rescued_data,_source_system,_source_entity,_source_file_path,_source_file_name,_source_file_size,_source_file_modification_time,_ingestion_timestamp,_ingestion_date,_record_hash
e1e32786504bf329dc6a2c4d80579a31,1,credit_card,7,345.94,null,olist,payments,/Volumes/dev_customer360/bronze/landing/olist/payments/olist_order_payments_dataset.csv,olist_order_payments_dataset.csv,5777138,2026-10-02T13:06:58.000Z,2026-10-02T13:26:34.354Z,2026-10-02,bfa64319232b8afd87a61b105b293b4c84d6562d54a9bc3e1fe327443b4ddb25
38cb813a638594505086f338bb5d4cae,1,credit_card,5,68.16,null,olist,payments,/Volumes/dev_customer360/bronze/landing/olist/payments/olist_order_payments_dataset.csv,olist_order_payments_dataset.csv,5777138,2026-10-02T13:06:58.000Z,2026-10-02T13:26:34.354Z,2026-10-02,8f6b118badb9ece219dd45c5e2045181c602c8af15216ae3e677515fe2f0ac73
ddb7a8a2786d0021954b09fd87426bec,1,credit_card,1,19.39,null,olist,payments,/Volumes/dev_customer360/bronze/landing/olist/payments/olist_order_payments_dataset.csv,olist_order_payments_dataset.csv,5777138,2026-10-02T13:06:58.000Z,2026-10-02T13:26:34.354Z,2026-10-02,7c01d17fb08f8600123475f0c0bd66a27870e8330197c7f710202f6019c6f133
a0f7769c320fd4c1900add6490eab094,1,credit_card,3,141.74,null,olist,payments,/Volumes/dev_customer360/bronze/landing/olist/payments/olist_order_payments_dataset.csv,olist_order_payments_dataset.csv,5777138,2026-10-02T13:06:58.000Z,2026-10-02T13:26:34.354Z,2026-10-02,967aed7aef7587604668b3c18dc1e6d94ad209e4053c924e9c155137f4ea09ec
e19633c5f388df807021cded7372d3bc,1,boleto,1,68.84,null,olist,payments,/Volumes/dev_customer360/bronze/landing/olist/payments/olist_order_payments_dataset.csv,olist_order_payments_dataset.csv,5777138,2026-10-02T13:06:58.000Z,2026-10-02T13:26:34.354Z,2026-10-02,b90ddd4f8c4d274a33af291594df8f6388521f04026024e9ad4995901e97d1f7
057c9f435d8e14fda9a72b7bbf8b381d,1,voucher,1,90.99,null,olist,payments,/Volumes/dev_customer360/bronze/landing/olist/payments/olist_order_payments_dataset.csv,olist_order_payments_dataset.csv,5777138,2026-10-02T13:06:58.000Z,2026-10-02T13:26:34.354Z,2026-10-02,473837ce66ad2b40875e7ed773dec587f6c696561d192b5f566c9a3f8cf0bebe
62da4cc6aa63ba0c28dd6418ceac3dbc,1,credit_card,10,266.01,null,olist,payments,/Volumes/dev_customer360/bronze/landing/olist/payments/olist_order_payments_dataset.csv,olist_order_payments_dataset.csv,5777138,2026-10-02T13:06:58.000Z,2026-10-02T13:26:34.354Z,2026-10-02,c3564dd0a4d84f80d826cb6a191b35cac8903ac6114ec7231813af805a4578e8
1bc2c38cb1ae7c211bef71067808a22f,1,credit_card,7,186.85,null,olist,payments,/Volumes/dev_customer360/bronze/landing/olist/payments/olist_order_payments_dataset.csv,olist_order_payments_dataset.csv,5777138,2026-10-02T13:06:58.000Z,2026-10-02T13:26:34.354Z,2026-10-02,9513e6b47db45693a0491c36c30f67b8f56eb3d79953fcc9d6b954208c42d0a4
1094e838b998a10c8faf3bc0b77906df,1,credit_card,3,83.74,null,olist,payments,/Volumes/dev_customer360/bronze/landing/olist/payments/olist_order_payments_dataset.csv,olist_order_payments_dataset.csv,5777138,2026-10-02T13:06:58.000Z,2026-10-02T13:26:34.354Z,2026-10-02,a44ad5239b12514dc41b3905f74de5a885fbc3f6de64bc831d4f858b7f3c78c6
b618ab0f426fbd3dd9dc8e184d33ce27,1,credit_card,6,466.16,null,olist,payments,/Volumes/dev_customer360/bronze/landing/olist/payments/olist_order_payments_dataset.csv,olist_order_payments_dataset.csv,5777138,2026-10-02T13:06:58.000Z,2026-10-02T13:26:34.354Z,2026-10-02,65b33d38d199ba983e0dcafb9315093f4d5156a950f07b7efaee1704c1d3949c


In [0]:
%sql
SELECT
    COUNT(*) AS orphan_payment_rows,
    COUNT(DISTINCT p.order_id) AS orphan_order_ids
FROM dev_customer360.bronze.bronze_payments p
LEFT ANTI JOIN dev_customer360.bronze.bronze_orders o
    ON p.order_id = o.order_id;

orphan_payment_rows,orphan_order_ids
0,0


In [0]:
from config.quality_rules import QUALITY_RULE_REGISTRY
from framework.quality_validator import QualityValidator

payments_df = spark.table(
    "dev_customer360.bronze.bronze_payments"
)

validator = QualityValidator()

validated_payments_df = validator.apply_rules(
    payments_df,
    QUALITY_RULE_REGISTRY["payments"]
)

validated_payments_df.groupBy(
    "_dq_status"
).count().show()

+----------+------+
|_dq_status| count|
+----------+------+
|     VALID|103886|
+----------+------+



In [0]:
%sql
SELECT
    _dq_status,
    COUNT(*) AS row_count
FROM dev_customer360.silver.validated_payments
GROUP BY _dq_status;

_dq_status,row_count
VALID,103886


In [0]:
%sql
SELECT
    (SELECT COUNT(*) FROM dev_customer360.bronze.bronze_payments) AS bronze_count,
    (SELECT COUNT(*) FROM dev_customer360.silver.validated_payments) AS eligible_count,
    (SELECT COUNT(*) FROM dev_customer360.ops.quarantine_payments) AS quarantine_count;

bronze_count,eligible_count,quarantine_count
103886,103886,0


In [0]:
%sql
SELECT
    COUNT(*) AS total_rows,

    COUNT_IF(review_id IS NULL) AS null_review_id,
    COUNT_IF(order_id IS NULL) AS null_order_id,

    COUNT_IF(review_score IS NULL) AS null_review_score,
    COUNT_IF(review_score < 1 OR review_score > 5)
        AS invalid_review_score,

    COUNT_IF(review_creation_date IS NULL)
        AS null_creation_date,

    COUNT_IF(review_answer_timestamp IS NULL)
        AS null_answer_timestamp,

    COUNT_IF(
        review_answer_timestamp IS NOT NULL
        AND review_creation_date IS NOT NULL
        AND review_answer_timestamp < review_creation_date
    ) AS answer_before_creation,

    COUNT_IF(_rescued_data IS NOT NULL)
        AS rescued_records

FROM dev_customer360.bronze.bronze_reviews;

total_rows,null_review_id,null_order_id,null_review_score,invalid_review_score,null_creation_date,null_answer_timestamp,answer_before_creation,rescued_records
99224,0,0,0,0,0,0,0,0


In [0]:
%sql
select * from dev_customer360.bronze.bronze_reviews

review_id,order_id,review_score,review_comment_title,review_comment_message,review_creation_date,review_answer_timestamp,_rescued_data,_source_system,_source_entity,_source_file_path,_source_file_name,_source_file_size,_source_file_modification_time,_ingestion_timestamp,_ingestion_date,_record_hash
7bc2406110b926393aa56f80a40eba40,73fc7af87114b39712e6da79b0a377eb,4,null,null,2018-01-18T00:00:00.000Z,2018-01-18T21:46:59.000Z,null,olist,reviews,/Volumes/dev_customer360/bronze/landing/olist/reviews/olist_order_reviews_dataset.csv,olist_order_reviews_dataset.csv,14451670,2026-10-02T13:06:59.000Z,2026-10-02T14:28:38.710Z,2026-10-02,32d125acc4c18321af2b9c181835ba53f7aa01bcdfb12ea769046fcaa3de83cb
80e641a11e56f04c1ad469d5645fdfde,a548910a1c6147796b98fdf73dbeba33,5,null,null,2018-03-10T00:00:00.000Z,2018-03-11T03:05:13.000Z,null,olist,reviews,/Volumes/dev_customer360/bronze/landing/olist/reviews/olist_order_reviews_dataset.csv,olist_order_reviews_dataset.csv,14451670,2026-10-02T13:06:59.000Z,2026-10-02T14:28:38.710Z,2026-10-02,aa20f8c22806d27412b8e14159977e6744ad324ff05ea386ef05b05b40fb25db
228ce5500dc1d8e020d8d1322874b6f0,f9e4b658b201a9f2ecdecbb34bed034b,5,null,null,2018-02-17T00:00:00.000Z,2018-02-18T14:36:24.000Z,null,olist,reviews,/Volumes/dev_customer360/bronze/landing/olist/reviews/olist_order_reviews_dataset.csv,olist_order_reviews_dataset.csv,14451670,2026-10-02T13:06:59.000Z,2026-10-02T14:28:38.710Z,2026-10-02,e5d92b1aa039ba02cbe8571b694bc1365cfc9b27f2f7fa168504c2f35ad06a63
e64fb393e7b32834bb789ff8bb30750e,658677c97b385a9be170737859d3511b,5,null,Recebi bem antes do prazo estipulado.,2017-04-21T00:00:00.000Z,2017-04-21T22:02:06.000Z,null,olist,reviews,/Volumes/dev_customer360/bronze/landing/olist/reviews/olist_order_reviews_dataset.csv,olist_order_reviews_dataset.csv,14451670,2026-10-02T13:06:59.000Z,2026-10-02T14:28:38.710Z,2026-10-02,f8fe48383288cc54b5f5207bfcd0c518adc14418525629dbcc0194cdb8ba3ee9
f7c4243c7fe1938f181bec41a392bdeb,8e6bfb81e283fa7e4f11123a3fb894f1,5,null,Parabéns lojas lannister adorei comprar pela Internet seguro e prático Parabéns a todos feliz Páscoa,2018-03-01T00:00:00.000Z,2018-03-02T10:26:53.000Z,null,olist,reviews,/Volumes/dev_customer360/bronze/landing/olist/reviews/olist_order_reviews_dataset.csv,olist_order_reviews_dataset.csv,14451670,2026-10-02T13:06:59.000Z,2026-10-02T14:28:38.710Z,2026-10-02,42036d1c909eb30530ca1d98fe7010848133b014646bffee5a9ac6edc6d39eed
15197aa66ff4d0650b5434f1b46cda19,b18dcdf73be66366873cd26c5724d1dc,1,null,null,2018-04-13T00:00:00.000Z,2018-04-16T00:39:37.000Z,null,olist,reviews,/Volumes/dev_customer360/bronze/landing/olist/reviews/olist_order_reviews_dataset.csv,olist_order_reviews_dataset.csv,14451670,2026-10-02T13:06:59.000Z,2026-10-02T14:28:38.710Z,2026-10-02,a72019261a366995fb285631cbf9aad0505ee4abf554766f9cd23be3d44530f2
07f9bee5d1b850860defd761afa7ff16,e48aa0d2dcec3a2e87348811bcfdf22b,5,null,null,2017-07-16T00:00:00.000Z,2017-07-18T19:30:34.000Z,null,olist,reviews,/Volumes/dev_customer360/bronze/landing/olist/reviews/olist_order_reviews_dataset.csv,olist_order_reviews_dataset.csv,14451670,2026-10-02T13:06:59.000Z,2026-10-02T14:28:38.710Z,2026-10-02,a555284cbceb532fea9b8b117e8f660f32b92ccd202412770bddb8270f6bcee6
7c6400515c67679fbee952a7525281ef,c31a859e34e3adac22f376954e19b39d,5,null,null,2018-08-14T00:00:00.000Z,2018-08-14T21:36:06.000Z,null,olist,reviews,/Volumes/dev_customer360/bronze/landing/olist/reviews/olist_order_reviews_dataset.csv,olist_order_reviews_dataset.csv,14451670,2026-10-02T13:06:59.000Z,2026-10-02T14:28:38.710Z,2026-10-02,b3799439d194d5ea8e3e6adda679474a6fcca133def45d6ade9c7ddfbd3b4a83
a3f6f7f6f433de0aefbb97da197c554c,9c214ac970e84273583ab523dfafd09b,5,null,null,2017-05-17T00:00:00.000Z,2017-05-18T12:05:37.000Z,null,olist,reviews,/Volumes/dev_customer360/bronze/landing/olist/reviews/olist_order_reviews_dataset.csv,olist_order_reviews_dataset.csv,14451670,2026-10-02T13:06:59.000Z,2026-10-02T14:28:38.710Z,2026-10-02,2ae0d1fc885e2ae4819fad320c0fff2689b7

In [0]:
%sql
SELECT
    COUNT(*) AS duplicate_key_groups,
    COALESCE(SUM(row_count - 1), 0) AS duplicate_rows
FROM (
    SELECT
        review_id,
        order_id,
        COUNT(*) AS row_count
    FROM dev_customer360.bronze.bronze_reviews
    GROUP BY
        review_id,
        order_id
    HAVING COUNT(*) > 1
);

duplicate_key_groups,duplicate_rows
0,0


In [0]:
%sql
SELECT
    COUNT(*) AS orphan_review_rows,
    COUNT(DISTINCT r.order_id) AS orphan_order_ids
FROM dev_customer360.bronze.bronze_reviews r
LEFT ANTI JOIN dev_customer360.bronze.bronze_orders o
    ON r.order_id = o.order_id;

orphan_review_rows,orphan_order_ids
0,0


In [0]:
import os
import sys

PROJECT_ROOT = os.path.abspath("..")

if PROJECT_ROOT not in sys.path:
    sys.path.insert(0, PROJECT_ROOT)

print(f"Project root: {PROJECT_ROOT}")

Project root: /Workspace/Users/karayatprabhakar@gmail.com/customer360


In [0]:
from config.quality_rules import QUALITY_RULE_REGISTRY
from framework.quality_validator import QualityValidator

reviews_df = spark.table(
    "dev_customer360.bronze.bronze_reviews"
)

validator = QualityValidator()

validated_reviews_df = validator.apply_rules(
    reviews_df,
    QUALITY_RULE_REGISTRY["reviews"]
)

validated_reviews_df.groupBy(
    "_dq_status"
).count().show()

+----------+-----+
|_dq_status|count|
+----------+-----+
|     VALID|99224|
+----------+-----+



In [0]:
%sql
SELECT
    (SELECT COUNT(*)
     FROM dev_customer360.bronze.bronze_reviews) AS bronze_count,
    (SELECT COUNT(*)
     FROM dev_customer360.silver.validated_reviews) AS eligible_count,
    (SELECT COUNT(*)
     FROM dev_customer360.ops.quarantine_reviews) AS quarantine_count;

bronze_count,eligible_count,quarantine_count
99224,99224,0


In [0]:
%sql
Select * from dev_customer360.bronze.bronze_products

product_id,product_category_name,product_name_lenght,product_description_lenght,product_photos_qty,product_weight_g,product_length_cm,product_height_cm,product_width_cm,_rescued_data,_source_system,_source_entity,_source_file_path,_source_file_name,_source_file_size,_source_file_modification_time,_ingestion_timestamp,_ingestion_date,_record_hash
42737e3759311804e830f222c6135e30,eletronicos,56,431,1,5950,98,17,18,null,olist,products,/Volumes/dev_customer360/bronze/landing/olist/products/olist_products_dataset.csv,olist_products_dataset.csv,2379446,2026-10-02T13:07:01.000Z,2026-10-02T13:26:29.346Z,2026-10-02,252bb9832b341e28d8ba48a7ae5a7184a2099b811507561a8ebe61e87cb7cfab
60f560fe3dd8adc165becf182ec8f834,esporte_lazer,48,236,2,3450,60,15,15,null,olist,products,/Volumes/dev_customer360/bronze/landing/olist/products/olist_products_dataset.csv,olist_products_dataset.csv,2379446,2026-10-02T13:07:01.000Z,2026-10-02T13:26:29.346Z,2026-10-02,583849980da03cc2888cbacb030189c1396d0b69221744f956ad923f5515a9d0
4b08796ea8ae2025d610f3e968e61471,papelaria,49,302,3,350,16,16,16,null,olist,products,/Volumes/dev_customer360/bronze/landing/olist/products/olist_products_dataset.csv,olist_products_dataset.csv,2379446,2026-10-02T13:07:01.000Z,2026-10-02T13:26:29.346Z,2026-10-02,f22b65045fe25e9a27523960c9a7f8ce00959d2f913a90d022e82d8d89ee375a
c8b5147de7ed25abf301f8138d4d07c7,automotivo,60,1351,2,1200,35,15,29,null,olist,products,/Volumes/dev_customer360/bronze/landing/olist/products/olist_products_dataset.csv,olist_products_dataset.csv,2379446,2026-10-02T13:07:01.000Z,2026-10-02T13:26:29.346Z,2026-10-02,b5ea4ad6ec85cb30b9caa1c233fd849801cc04e4098ffc889c173df847d2fadf
008b0ec3de3638637099f97add750136,beleza_saude,48,516,1,690,17,17,13,null,olist,products,/Volumes/dev_customer360/bronze/landing/olist/products/olist_products_dataset.csv,olist_products_dataset.csv,2379446,2026-10-02T13:07:01.000Z,2026-10-02T13:26:29.346Z,2026-10-02,56821f8a5b3935ae3a7f50449d9bb841fe1ee6c8e7c3f3c1a57c3c63bf3643e2
9060e6841dc01d7b51ec7e7b173ede4e,papelaria,60,127,3,2900,25,55,45,null,olist,products,/Volumes/dev_customer360/bronze/landing/olist/products/olist_products_dataset.csv,olist_products_dataset.csv,2379446,2026-10-02T13:07:01.000Z,2026-10-02T13:26:29.346Z,2026-10-02,14964b76f428766a40d609585818762a3f8ea0209d4370f4f0d5526bab2c6585
773fc6de13d1f04a533ab4186b52420a,bebes,60,2135,3,1550,42,30,37,null,olist,products,/Volumes/dev_customer360/bronze/landing/olist/products/olist_products_dataset.csv,olist_products_dataset.csv,2379446,2026-10-02T13:07:01.000Z,2026-10-02T13:26:29.346Z,2026-10-02,d02fa2eb266912efbee9f65f445f231a6839897a478ad3b150ae0714ab82f9b7
f1b1c272713f21efd25aec03865dffe3,moveis_decoracao,45,713,4,600,34,6,23,null,olist,products,/Volumes/dev_customer360/bronze/landing/olist/products/olist_products_dataset.csv,olist_products_dataset.csv,2379446,2026-10-02T13:07:01.000Z,2026-10-02T13:26:29.346Z,2026-10-02,6fa32419eadbd9016b38454fef0d76f1ee19ed87616f2b00b4df591e6aa5eba3
c5f5b4b17e4cd989c39986cd0dddc018,moveis_decoracao,55,329,2,350,16,16,16,null,olist,products,/Volumes/dev_customer360/bronze/landing/olist/products/olist_products_dataset.csv,olist_products_dataset.csv,2379446,2026-10-02T13:07:01.000Z,2026-10-02T13:26:29.346Z,2026-10-02,f210fe8cf1c11dcb3581856327b7fea8999d44d3f6ce1e1a3e2a9a0168b4cc46
e311d1899b83ab4b7706f6f81d155a19,papelaria,54,223,4,1500,60,20,29,null,olist,products,/Volumes/dev_customer360/bronze/landing/olist/products/olist_products_dataset.csv,olist_products_dataset.csv,2379446,2026-10-02T13:07:01.000Z,2026-10-02T13:26:29.346Z,2026-10-02,1d174a70619c2a4acc5f1770df9fb415e0335626be67824158ed2404e0b793ef


In [0]:
%sql
SELECT
    COUNT(*) AS total_rows,
    COUNT_IF(product_id IS NULL) AS null_product_id,
    COUNT_IF(
        product_category_name IS NULL
        OR TRIM(product_category_name) = ''
    ) AS null_or_blank_category,

    COUNT_IF(product_name_lenght IS NULL)
        AS null_name_length,

    COUNT_IF(product_description_lenght IS NULL)
        AS null_description_length,

    COUNT_IF(product_photos_qty IS NULL)
        AS null_photos_qty,

    COUNT_IF(product_weight_g IS NULL)
        AS null_weight,

    COUNT_IF(product_length_cm IS NULL)
        AS null_length,

    COUNT_IF(product_height_cm IS NULL)
        AS null_height,

    COUNT_IF(product_width_cm IS NULL)
        AS null_width,

    COUNT_IF(
        product_weight_g <= 0
        OR product_length_cm <= 0
        OR product_height_cm <= 0
        OR product_width_cm <= 0
    ) AS non_positive_dimensions,

    COUNT_IF(_rescued_data IS NOT NULL)
        AS rescued_records

FROM dev_customer360.bronze.bronze_products;

total_rows,null_product_id,null_or_blank_category,null_name_length,null_description_length,null_photos_qty,null_weight,null_length,null_height,null_width,non_positive_dimensions,rescued_records
32951,0,610,610,610,610,2,2,2,2,4,0


In [0]:
%sql
SELECT
    COUNT(*) AS rows_with_any_metadata_null,

    COUNT_IF(
        product_category_name IS NULL
        AND product_name_lenght IS NULL
        AND product_description_lenght IS NULL
        AND product_photos_qty IS NULL
    ) AS rows_with_all_metadata_null,

    COUNT_IF(
        product_category_name IS NULL
        AND (
            product_name_lenght IS NOT NULL
            OR product_description_lenght IS NOT NULL
            OR product_photos_qty IS NOT NULL
        )
    ) AS category_only_or_partial_null,

    COUNT_IF(
        product_category_name IS NOT NULL
        AND (
            product_name_lenght IS NULL
            OR product_description_lenght IS NULL
            OR product_photos_qty IS NULL
        )
    ) AS attributes_null_but_category_present

FROM dev_customer360.bronze.bronze_products

WHERE
       product_category_name IS NULL
    OR product_name_lenght IS NULL
    OR product_description_lenght IS NULL
    OR product_photos_qty IS NULL;

rows_with_any_metadata_null,rows_with_all_metadata_null,category_only_or_partial_null,attributes_null_but_category_present
610,610,0,0


In [0]:
%sql
SELECT
    product_id,
    product_category_name,
    product_weight_g,
    product_length_cm,
    product_height_cm,
    product_width_cm
FROM dev_customer360.bronze.bronze_products
WHERE
       product_weight_g IS NULL
    OR product_length_cm IS NULL
    OR product_height_cm IS NULL
    OR product_width_cm IS NULL
    OR product_weight_g <= 0
    OR product_length_cm <= 0
    OR product_height_cm <= 0
    OR product_width_cm <= 0
ORDER BY product_id;

product_id,product_category_name,product_weight_g,product_length_cm,product_height_cm,product_width_cm
09ff539a621711667c43eba6a3bd8466,bebes,null,null,null,null
36ba42dd187055e1fbe943b2d11430ca,cama_mesa_banho,0,30,25,30
5eb564652db742ff8f28759cd8d2652a,null,null,null,null,null
8038040ee2a71048d4bdbbdc985b69ab,cama_mesa_banho,0,30,25,30
81781c0fed9fe1ad6e8c81fca1e1cb08,cama_mesa_banho,0,30,25,30
e673e90efa65a5409ff4196c038bb5af,cama_mesa_banho,0,30,25,30


In [0]:
%sql
SELECT
    p.product_id,
    p.product_category_name,
    p.product_weight_g,
    p.product_length_cm,
    p.product_height_cm,
    p.product_width_cm,

    COUNT(oi.order_id) AS order_item_rows,
    COUNT(DISTINCT oi.order_id) AS distinct_orders,
    ROUND(SUM(oi.price), 2) AS total_item_value

FROM dev_customer360.bronze.bronze_products p

LEFT JOIN dev_customer360.bronze.bronze_order_items oi
    ON p.product_id = oi.product_id

WHERE
       p.product_weight_g IS NULL
    OR p.product_length_cm IS NULL
    OR p.product_height_cm IS NULL
    OR p.product_width_cm IS NULL
    OR p.product_weight_g <= 0
    OR p.product_length_cm <= 0
    OR p.product_height_cm <= 0
    OR p.product_width_cm <= 0

GROUP BY
    p.product_id,
    p.product_category_name,
    p.product_weight_g,
    p.product_length_cm,
    p.product_height_cm,
    p.product_width_cm

ORDER BY p.product_id;

product_id,product_category_name,product_weight_g,product_length_cm,product_height_cm,product_width_cm,order_item_rows,distinct_orders,total_item_value
09ff539a621711667c43eba6a3bd8466,bebes,null,null,null,null,1,1,1934.0
36ba42dd187055e1fbe943b2d11430ca,cama_mesa_banho,0,30,25,30,2,1,200.0
5eb564652db742ff8f28759cd8d2652a,null,null,null,null,null,17,15,563.0
8038040ee2a71048d4bdbbdc985b69ab,cama_mesa_banho,0,30,25,30,1,1,129.9
81781c0fed9fe1ad6e8c81fca1e1cb08,cama_mesa_banho,0,30,25,30,1,1,100.0
e673e90efa65a5409ff4196c038bb5af,cama_mesa_banho,0,30,25,30,4,3,519.6


In [0]:
%sql
SELECT
    COUNT(*) AS duplicate_product_id_groups,
    COALESCE(SUM(row_count - 1), 0) AS duplicate_product_rows
FROM (
    SELECT
        product_id,
        COUNT(*) AS row_count
    FROM dev_customer360.bronze.bronze_products
    GROUP BY product_id
    HAVING COUNT(*) > 1
);

duplicate_product_id_groups,duplicate_product_rows
0,0


In [0]:
from config.quality_rules import QUALITY_RULE_REGISTRY
from framework.quality_validator import QualityValidator

products_df = spark.table(
    "dev_customer360.bronze.bronze_products"
)

validator = QualityValidator()

validated_products_df = validator.apply_rules(
    products_df,
    QUALITY_RULE_REGISTRY["products"]
)

validated_products_df.groupBy(
    "_dq_status"
).count().show()

+----------+-----+
|_dq_status|count|
+----------+-----+
|     VALID|32945|
|   WARNING|    6|
+----------+-----+



In [0]:
%sql 
SELECT
    (SELECT COUNT(*)
     FROM dev_customer360.bronze.bronze_products) AS bronze_count,
    (SELECT COUNT(*)
     FROM dev_customer360.silver.validated_products) AS eligible_count,
    (SELECT COUNT(*)
     FROM dev_customer360.ops.quarantine_products) AS quarantine_count,
    (SELECT COUNT(*)
     FROM dev_customer360.silver.validated_products
     WHERE _dq_status = 'VALID') AS valid_count,
    (SELECT COUNT(*)
     FROM dev_customer360.silver.validated_products
     WHERE _dq_status = 'WARNING') AS warning_count;

bronze_count,eligible_count,quarantine_count,valid_count,warning_count
32951,32951,0,32945,6


In [0]:
%sql
SELECT
    COUNT(*) AS total_rows,
    COUNT_IF(seller_id IS NULL)
        AS null_seller_id,
    COUNT_IF(seller_zip_code_prefix IS NULL)
        AS null_zip,
    COUNT_IF(
        seller_city IS NULL
        OR TRIM(seller_city) = ''
    ) AS null_or_blank_city,
    COUNT_IF(
        seller_state IS NULL
        OR TRIM(seller_state) = ''
    ) AS null_or_blank_state,
    COUNT_IF(
        seller_state IS NOT NULL
        AND NOT seller_state RLIKE '^[A-Z]{2}$'
    ) AS invalid_state_format,
    COUNT_IF(_rescued_data IS NOT NULL)
        AS rescued_records
FROM dev_customer360.bronze.bronze_sellers;

total_rows,null_seller_id,null_zip,null_or_blank_city,null_or_blank_state,invalid_state_format,rescued_records
3095,0,0,0,0,0,0


In [0]:
%sql
SELECT
    COUNT(*) AS duplicate_seller_id_groups,
    COALESCE(SUM(row_count - 1), 0) AS duplicate_seller_rows
FROM (
    SELECT
        seller_id,
        COUNT(*) AS row_count
    FROM dev_customer360.bronze.bronze_sellers
    GROUP BY seller_id
    HAVING COUNT(*) > 1
);

duplicate_seller_id_groups,duplicate_seller_rows
0,0


In [0]:
%sql
SELECT
    COUNT(*) AS orphan_order_item_rows,
    COUNT(DISTINCT oi.seller_id) AS orphan_seller_ids
FROM dev_customer360.bronze.bronze_order_items oi
LEFT ANTI JOIN dev_customer360.bronze.bronze_sellers s
    ON oi.seller_id = s.seller_id;

orphan_order_item_rows,orphan_seller_ids
0,0


In [0]:
from config.quality_rules import QUALITY_RULE_REGISTRY
from framework.quality_validator import QualityValidator

sellers_df = spark.table(
    "dev_customer360.bronze.bronze_sellers"
)

validator = QualityValidator()

validated_sellers_df = validator.apply_rules(
    sellers_df,
    QUALITY_RULE_REGISTRY["sellers"]
)

validated_sellers_df.groupBy(
    "_dq_status"
).count().show()

+----------+-----+
|_dq_status|count|
+----------+-----+
|     VALID| 3095|
+----------+-----+



In [0]:
%sql
SELECT
    (SELECT COUNT(*)
     FROM dev_customer360.bronze.bronze_sellers) AS bronze_count,

    (SELECT COUNT(*)
     FROM dev_customer360.silver.validated_sellers) AS eligible_count,

    (SELECT COUNT(*)
     FROM dev_customer360.ops.quarantine_sellers) AS quarantine_count,

    (SELECT COUNT(*)
     FROM dev_customer360.silver.validated_sellers
     WHERE _dq_status = 'VALID') AS valid_count;

bronze_count,eligible_count,quarantine_count,valid_count
3095,3095,0,3095


In [0]:
%sql
Select * from dev_customer360.bronze.bronze_geolocation;

SELECT
    COUNT(*) AS total_rows,
    COUNT_IF(geolocation_zip_code_prefix IS NULL) AS null_zip,
    COUNT_IF(geolocation_lat IS NULL) AS null_latitude,
    COUNT_IF(geolocation_lng IS NULL) AS null_longitude,
    COUNT_IF(geolocation_city IS NULL OR TRIM(geolocation_city) = '') AS null_or_blank_city,
    
    COUNT_IF(geolocation_state IS NULL OR TRIM(geolocation_state) = '') AS null_or_blank_state,
    
    COUNT_IF(geolocation_lat IS NOT NULL AND (geolocation_lat < -90 OR geolocation_lat > 90)) AS invalid_latitude,
    
    COUNT_IF(geolocation_lng IS NOT NULL AND (geolocation_lng < -180 OR geolocation_lng > 180)) AS invalid_longitude,

    COUNT_IF(geolocation_state IS NOT NULL AND NOT geolocation_state RLIKE '^[A-Z]{2}$') AS invalid_state_format,
    COUNT_IF(_rescued_data IS NOT NULL) AS rescued_records
FROM dev_customer360.bronze.bronze_geolocation;

total_rows,null_zip,null_latitude,null_longitude,null_or_blank_city,null_or_blank_state,invalid_latitude,invalid_longitude,invalid_state_format,rescued_records
1000163,0,0,0,0,0,0,0,0,0


In [0]:
%sql
WITH zip_counts AS (
    SELECT
        geolocation_zip_code_prefix,
        COUNT(*) AS zip_row_count
    FROM dev_customer360.bronze.bronze_geolocation
    GROUP BY geolocation_zip_code_prefix
)

SELECT
    COUNT(*) AS distinct_zip_codes,
    SUM(zip_row_count) AS total_geolocation_rows,
    SUM(zip_row_count) - COUNT(*) AS additional_rows_beyond_unique_zip,
    MAX(zip_row_count) AS max_rows_for_single_zip,
    ROUND(AVG(zip_row_count), 2) AS avg_rows_per_zip
FROM zip_counts;

distinct_zip_codes,total_geolocation_rows,additional_rows_beyond_unique_zip,max_rows_for_single_zip,avg_rows_per_zip
19015,1000163,981148,1146,52.6


In [0]:
%sql
WITH zip_profile AS (
    SELECT
        geolocation_zip_code_prefix,
        COUNT(DISTINCT geolocation_city) AS distinct_cities,
        COUNT(DISTINCT geolocation_state) AS distinct_states
    FROM dev_customer360.bronze.bronze_geolocation
    GROUP BY geolocation_zip_code_prefix
)

SELECT
    COUNT(*) AS total_zip_codes,
    COUNT_IF(distinct_cities > 1) AS zips_with_multiple_cities,
    COUNT_IF(distinct_states > 1) AS zips_with_multiple_states,
    MAX(distinct_cities) AS max_cities_per_zip,
    MAX(distinct_states) AS max_states_per_zip
FROM zip_profile;

total_zip_codes,zips_with_multiple_cities,zips_with_multiple_states,max_cities_per_zip,max_states_per_zip
19015,8556,8,5,2


In [0]:
%sql
WITH multi_state_zips AS (
    SELECT
        geolocation_zip_code_prefix
    FROM dev_customer360.bronze.bronze_geolocation
    GROUP BY geolocation_zip_code_prefix
    HAVING COUNT(DISTINCT geolocation_state) > 1
)

SELECT
    g.geolocation_zip_code_prefix,
    g.geolocation_state,
    COUNT(*) AS observation_count,
    COUNT(DISTINCT g.geolocation_city) AS distinct_cities,
    MIN(g.geolocation_city) AS sample_city
FROM dev_customer360.bronze.bronze_geolocation g

INNER JOIN multi_state_zips m
    ON g.geolocation_zip_code_prefix =
       m.geolocation_zip_code_prefix

GROUP BY
    g.geolocation_zip_code_prefix,
    g.geolocation_state

ORDER BY
    g.geolocation_zip_code_prefix,
    observation_count DESC;

geolocation_zip_code_prefix,geolocation_state,observation_count,distinct_cities,sample_city
2116,SP,12,2,sao paulo
2116,RN,1,1,são paulo
4011,SP,178,2,sao paulo
4011,AC,1,1,sao paulo
21550,RJ,170,1,rio de janeiro
21550,AC,1,1,rio de janeiro
23056,RJ,60,1,rio de janeiro
23056,AC,1,1,rio de janeiro
72915,GO,40,2,aguas lindas de goias
72915,DF,1,1,taguatinga


In [0]:
%sql
WITH multi_city_zips AS (
    SELECT
        geolocation_zip_code_prefix,
        COUNT(DISTINCT geolocation_city) AS city_count,
        COUNT(*) AS total_observations
    FROM dev_customer360.bronze.bronze_geolocation
    GROUP BY geolocation_zip_code_prefix
    HAVING COUNT(DISTINCT geolocation_city) > 1
),

top_zips AS (
    SELECT *
    FROM multi_city_zips
    ORDER BY total_observations DESC
    LIMIT 10
)

SELECT
    g.geolocation_zip_code_prefix,
    g.geolocation_city,
    g.geolocation_state,
    COUNT(*) AS observation_count
FROM dev_customer360.bronze.bronze_geolocation g

INNER JOIN top_zips t
    ON g.geolocation_zip_code_prefix =
       t.geolocation_zip_code_prefix

GROUP BY
    g.geolocation_zip_code_prefix,
    g.geolocation_city,
    g.geolocation_state

ORDER BY
    g.geolocation_zip_code_prefix,
    observation_count DESC;

geolocation_zip_code_prefix,geolocation_city,geolocation_state,observation_count
11740,itanhaem,SP,669
11740,itanhaém,SP,119
24220,niteroi,RJ,997
24220,niterói,RJ,149
24230,niteroi,RJ,969
24230,niterói,RJ,133
35500,divinopolis,MG,775
35500,divinópolis,MG,132
36570,vicosa,MG,607
36570,viçosa,MG,60


In [0]:
%sql
WITH duplicate_groups AS (
    SELECT
        geolocation_zip_code_prefix,
        geolocation_lat,
        geolocation_lng,
        geolocation_city,
        geolocation_state,
        COUNT(*) AS row_count

    FROM dev_customer360.bronze.bronze_geolocation

    GROUP BY
        geolocation_zip_code_prefix,
        geolocation_lat,
        geolocation_lng,
        geolocation_city,
        geolocation_state

    HAVING COUNT(*) > 1
)

SELECT
    COUNT(*) AS exact_duplicate_groups,

    COALESCE(
        SUM(row_count - 1),
        0
    ) AS additional_duplicate_rows

FROM duplicate_groups;

exact_duplicate_groups,additional_duplicate_rows
128174,261831


In [0]:
%sql
WITH geo_zips AS (
    SELECT DISTINCT geolocation_zip_code_prefix AS zip_code
    FROM dev_customer360.bronze.bronze_geolocation
),

customer_zip_check AS (
    SELECT
        COUNT(*) AS orphan_customer_rows,
        COUNT(DISTINCT c.customer_zip_code_prefix) AS orphan_customer_zips
    FROM dev_customer360.bronze.bronze_customers c
    LEFT ANTI JOIN geo_zips g
        ON c.customer_zip_code_prefix = g.zip_code
    WHERE c.customer_zip_code_prefix IS NOT NULL
),

seller_zip_check AS (
    SELECT
        COUNT(*) AS orphan_seller_rows,
        COUNT(DISTINCT s.seller_zip_code_prefix) AS orphan_seller_zips
    FROM dev_customer360.bronze.bronze_sellers s
    LEFT ANTI JOIN geo_zips g
        ON s.seller_zip_code_prefix = g.zip_code
    WHERE s.seller_zip_code_prefix IS NOT NULL
)

SELECT
    c.orphan_customer_rows,
    c.orphan_customer_zips,
    s.orphan_seller_rows,
    s.orphan_seller_zips
FROM customer_zip_check c
CROSS JOIN seller_zip_check s;

orphan_customer_rows,orphan_customer_zips,orphan_seller_rows,orphan_seller_zips
282,161,7,7


In [0]:
import os
import sys

PROJECT_ROOT = os.path.abspath("..")

if PROJECT_ROOT not in sys.path:
    sys.path.insert(0, PROJECT_ROOT)

print(f"Project root: {PROJECT_ROOT}") 

Project root: /Workspace/Users/karayatprabhakar@gmail.com/customer360


In [0]:
from config.quality_rules import QUALITY_RULE_REGISTRY
from framework.quality_validator import QualityValidator

geolocation_df = spark.table(
    "dev_customer360.bronze.bronze_geolocation"
)

validator = QualityValidator()

validated_geolocation_df = validator.apply_rules(
    geolocation_df,
    QUALITY_RULE_REGISTRY["geolocation"]
)

validated_geolocation_df.groupBy(
    "_dq_status"
).count().show()

+----------+-------+
|_dq_status|  count|
+----------+-------+
|     VALID|1000163|
+----------+-------+



In [0]:
%sql
SELECT
    (SELECT COUNT(*)
     FROM dev_customer360.bronze.bronze_geolocation) AS bronze_count,

    (SELECT COUNT(*)
     FROM dev_customer360.silver.validated_geolocation) AS eligible_count,

    (SELECT COUNT(*)
     FROM dev_customer360.ops.quarantine_geolocation) AS quarantine_count,

    (SELECT COUNT(*)
     FROM dev_customer360.silver.validated_geolocation
     WHERE _dq_status = 'VALID') AS valid_count;

bronze_count,eligible_count,quarantine_count,valid_count
1000163,1000163,0,1000163


In [0]:
%sql
SELECT
    COUNT(*) AS total_rows,

    COUNT_IF(product_category_name IS NULL)
        AS null_category_name,

    COUNT_IF(
        product_category_name IS NOT NULL
        AND TRIM(product_category_name) = ''
    ) AS blank_category_name,

    COUNT_IF(product_category_name_english IS NULL)
        AS null_english_name,

    COUNT_IF(
        product_category_name_english IS NOT NULL
        AND TRIM(product_category_name_english) = ''
    ) AS blank_english_name,

    COUNT_IF(_rescued_data IS NOT NULL)
        AS rescued_records

FROM dev_customer360.bronze.bronze_category_translation;

total_rows,null_category_name,blank_category_name,null_english_name,blank_english_name,rescued_records
71,0,0,0,0,0


In [0]:
%sql
SELECT
    COUNT(*) AS duplicate_category_groups,
    COALESCE(SUM(row_count - 1), 0) AS duplicate_category_rows
FROM (
    SELECT
        product_category_name,
        COUNT(*) AS row_count
    FROM dev_customer360.bronze.bronze_category_translation
    GROUP BY product_category_name
    HAVING COUNT(*) > 1
);

duplicate_category_groups,duplicate_category_rows
0,0


In [0]:
%sql
SELECT
    COUNT(*) AS products_without_translation,
    COUNT(DISTINCT p.product_category_name)
        AS distinct_categories_without_translation

FROM dev_customer360.bronze.bronze_products p

LEFT ANTI JOIN dev_customer360.bronze.bronze_category_translation t
    ON p.product_category_name = t.product_category_name

WHERE p.product_category_name IS NOT NULL
  AND TRIM(p.product_category_name) <> '';

products_without_translation,distinct_categories_without_translation
13,2


In [0]:
%sql
SELECT
    p.product_category_name,
    COUNT(*) AS product_count
FROM dev_customer360.bronze.bronze_products p

LEFT ANTI JOIN dev_customer360.bronze.bronze_category_translation t
    ON p.product_category_name = t.product_category_name

WHERE p.product_category_name IS NOT NULL
  AND TRIM(p.product_category_name) <> ''

GROUP BY p.product_category_name
ORDER BY product_count DESC;

product_category_name,product_count
portateis_cozinha_e_preparadores_de_alimentos,10
pc_gamer,3


In [0]:
from config.quality_rules import QUALITY_RULE_REGISTRY
from framework.quality_validator import QualityValidator

category_translation_df = spark.table(
    "dev_customer360.bronze.bronze_category_translation"
)

validator = QualityValidator()

validated_category_translation_df = validator.apply_rules(
    category_translation_df,
    QUALITY_RULE_REGISTRY["category_translation"]
)

validated_category_translation_df.groupBy(
    "_dq_status"
).count().show()

+----------+-----+
|_dq_status|count|
+----------+-----+
|     VALID|   71|
+----------+-----+



In [0]:
%sql
SELECT
    (SELECT COUNT(*)
     FROM dev_customer360.bronze.bronze_category_translation)
        AS bronze_count,

    (SELECT COUNT(*)
     FROM dev_customer360.silver.validated_category_translation)
        AS eligible_count,

    (SELECT COUNT(*)
     FROM dev_customer360.ops.quarantine_category_translation)
        AS quarantine_count,

    (SELECT COUNT(*)
     FROM dev_customer360.silver.validated_category_translation
     WHERE _dq_status = 'VALID')
        AS valid_count;

bronze_count,eligible_count,quarantine_count,valid_count
71,71,0,71


In [0]:
%sql
SELECT
    entity,
    bronze_count,
    eligible_count,
    quarantine_count,
    bronze_count - (eligible_count + quarantine_count) AS reconciliation_diff,
    CASE
        WHEN bronze_count = eligible_count + quarantine_count
        THEN 'PASS'
        ELSE 'FAIL'
    END AS reconciliation_status
FROM (
    SELECT
        'customers' AS entity,
        (SELECT COUNT(*) FROM dev_customer360.bronze.bronze_customers) AS bronze_count,
        (SELECT COUNT(*) FROM dev_customer360.silver.validated_customers) AS eligible_count,
        (SELECT COUNT(*) FROM dev_customer360.ops.quarantine_customers) AS quarantine_count
    UNION ALL
    SELECT
        'orders',
        (SELECT COUNT(*) FROM dev_customer360.bronze.bronze_orders),
        (SELECT COUNT(*) FROM dev_customer360.silver.validated_orders),
        (SELECT COUNT(*) FROM dev_customer360.ops.quarantine_orders)
    UNION ALL
    SELECT
        'order_items',
        (SELECT COUNT(*) FROM dev_customer360.bronze.bronze_order_items),
        (SELECT COUNT(*) FROM dev_customer360.silver.validated_order_items),
        (SELECT COUNT(*) FROM dev_customer360.ops.quarantine_order_items)
    UNION ALL
    SELECT
        'payments',
        (SELECT COUNT(*) FROM dev_customer360.bronze.bronze_payments),
        (SELECT COUNT(*) FROM dev_customer360.silver.validated_payments),
        (SELECT COUNT(*) FROM dev_customer360.ops.quarantine_payments)
    UNION ALL
    SELECT
        'reviews',
        (SELECT COUNT(*) FROM dev_customer360.bronze.bronze_reviews),
        (SELECT COUNT(*) FROM dev_customer360.silver.validated_reviews),
        (SELECT COUNT(*) FROM dev_customer360.ops.quarantine_reviews)
    UNION ALL
    SELECT
        'products',
        (SELECT COUNT(*) FROM dev_customer360.bronze.bronze_products),
        (SELECT COUNT(*) FROM dev_customer360.silver.validated_products),
        (SELECT COUNT(*) FROM dev_customer360.ops.quarantine_products)
    UNION ALL
    SELECT
        'sellers',
        (SELECT COUNT(*) FROM dev_customer360.bronze.bronze_sellers),
        (SELECT COUNT(*) FROM dev_customer360.silver.validated_sellers),
        (SELECT COUNT(*) FROM dev_customer360.ops.quarantine_sellers)
    UNION ALL
    SELECT
        'geolocation',
        (SELECT COUNT(*) FROM dev_customer360.bronze.bronze_geolocation),
        (SELECT COUNT(*) FROM dev_customer360.silver.validated_geolocation),
        (SELECT COUNT(*) FROM dev_customer360.ops.quarantine_geolocation)
    UNION ALL
    SELECT
        'category_translation',
        (SELECT COUNT(*) FROM dev_customer360.bronze.bronze_category_translation),
        (SELECT COUNT(*) FROM dev_customer360.silver.validated_category_translation),
        (SELECT COUNT(*) FROM dev_customer360.ops.quarantine_category_translation)

);

entity,bronze_count,eligible_count,quarantine_count,reconciliation_diff,reconciliation_status
customers,99446,99443,3,0,PASS
orders,99441,99441,0,0,PASS
order_items,112650,112650,0,0,PASS
payments,103886,103886,0,0,PASS
reviews,99224,99224,0,0,PASS
products,32951,32951,0,0,PASS
sellers,3095,3095,0,0,PASS
geolocation,1000163,1000163,0,0,PASS
category_translation,71,71,0,0,PASS


In [0]:
%sql
WITH customer_identity_profile AS (
    SELECT
        customer_unique_id,
        COUNT(*) AS customer_id_count
    FROM dev_customer360.silver.validated_customers
    GROUP BY customer_unique_id
)

SELECT
    COUNT(*) AS unique_customers,

    COUNT_IF(customer_id_count = 1)
        AS customers_with_one_customer_id,

    COUNT_IF(customer_id_count > 1)
        AS customers_with_multiple_customer_ids,

    MAX(customer_id_count)
        AS max_customer_ids_per_customer,

    ROUND(AVG(customer_id_count), 2)
        AS avg_customer_ids_per_customer

FROM customer_identity_profile;

unique_customers,customers_with_one_customer_id,customers_with_multiple_customer_ids,max_customer_ids_per_customer,avg_customer_ids_per_customer
96098,93101,2997,17,1.03


In [0]:
%sql

WITH customer_profile AS (
    SELECT
        customer_unique_id,

        COUNT(*) AS customer_id_count,

        COUNT(DISTINCT customer_zip_code_prefix)
            AS distinct_zip_count,

        COUNT(DISTINCT customer_city)
            AS distinct_city_count,

        COUNT(DISTINCT customer_state)
            AS distinct_state_count

    FROM dev_customer360.silver.validated_customers

    GROUP BY customer_unique_id
)

SELECT
    COUNT_IF(customer_id_count > 1)
        AS repeat_customers,

    COUNT_IF(
        customer_id_count > 1
        AND distinct_zip_count > 1
    ) AS repeat_customers_with_multiple_zips,

    COUNT_IF(
        customer_id_count > 1
        AND distinct_city_count > 1
    ) AS repeat_customers_with_multiple_cities,

    COUNT_IF(
        customer_id_count > 1
        AND distinct_state_count > 1
    ) AS repeat_customers_with_multiple_states,

    MAX(distinct_zip_count)
        AS max_zips_per_customer,

    MAX(distinct_city_count)
        AS max_cities_per_customer,

    MAX(distinct_state_count)
        AS max_states_per_customer

FROM customer_profile;

repeat_customers,repeat_customers_with_multiple_zips,repeat_customers_with_multiple_cities,repeat_customers_with_multiple_states,max_zips_per_customer,max_cities_per_customer,max_states_per_customer
2997,250,122,39,3,3,3


In [0]:
%sql
SELECT
    COUNT(*) AS customer_rows,
    COUNT(o.order_id) AS customer_rows_with_order,
    COUNT_IF(o.order_id IS NULL)
        AS customer_rows_without_order,
    COUNT_IF(o.order_purchase_timestamp IS NULL)
        AS customer_rows_without_purchase_timestamp,
    COUNT_IF(o.order_id IS NOT NULL)
        - COUNT(DISTINCT c.customer_id)
        AS potential_extra_order_mappings
FROM dev_customer360.silver.validated_customers c
LEFT JOIN dev_customer360.silver.validated_orders o
    ON c.customer_id = o.customer_id;

customer_rows,customer_rows_with_order,customer_rows_without_order,customer_rows_without_purchase_timestamp,potential_extra_order_mappings
99443,99441,2,2,-2


In [0]:
%sql
WITH customer_order_mapping AS (
    SELECT
        c.customer_id,
        COUNT(o.order_id) AS order_count
    FROM dev_customer360.silver.validated_customers c

    LEFT JOIN dev_customer360.silver.validated_orders o
        ON c.customer_id = o.customer_id

    GROUP BY c.customer_id
)

SELECT
    COUNT_IF(order_count = 0) AS customer_ids_without_order,
    COUNT_IF(order_count = 1) AS customer_ids_with_one_order,
    COUNT_IF(order_count > 1) AS customer_ids_with_multiple_orders,
    MAX(order_count) AS max_orders_per_customer_id
FROM customer_order_mapping;

customer_ids_without_order,customer_ids_with_one_order,customer_ids_with_multiple_orders,max_orders_per_customer_id
2,99441,0,1


In [0]:
%sql
WITH customer_history AS (
    SELECT
        c.customer_unique_id,
        c.customer_id,
        c.customer_zip_code_prefix,
        c.customer_city,
        c.customer_state,
        o.order_id,
        o.order_purchase_timestamp,
        ROW_NUMBER() OVER (
            PARTITION BY c.customer_unique_id
            ORDER BY o.order_purchase_timestamp
        ) AS observation_sequence
    FROM dev_customer360.silver.validated_customers c
    INNER JOIN dev_customer360.silver.validated_orders o
        ON c.customer_id = o.customer_id
),
changed_customers AS (
    SELECT customer_unique_id
    FROM customer_history
    GROUP BY customer_unique_id
    HAVING COUNT(DISTINCT customer_zip_code_prefix) > 1
)
SELECT
    h.customer_unique_id,
    h.observation_sequence,
    h.customer_id,
    h.order_id,
    h.order_purchase_timestamp,
    h.customer_zip_code_prefix,
    h.customer_city,
    h.customer_state
FROM customer_history h
INNER JOIN changed_customers c
    ON h.customer_unique_id = c.customer_unique_id
ORDER BY
    h.customer_unique_id,
    h.observation_sequence
LIMIT 30;

customer_unique_id,observation_sequence,customer_id,order_id,order_purchase_timestamp,customer_zip_code_prefix,customer_city,customer_state
004b45ec5c64187465168251cd1c9c2f,1,49cf243e0d353cd418ca77868e24a670,90ae229a4addcfead792e2564554f09c,2017-09-01T12:11:23.000Z,57055,maceio,AL
004b45ec5c64187465168251cd1c9c2f,2,d95f60d70d9ea9a7fe37c53c931940bb,9392c5e72885ad5aba87e6223ca9838d,2018-05-26T19:42:48.000Z,57035,maceio,AL
0058f300f57d7b93c477a131a59b36c3,1,f530197ea86ced9488a03d055e118ebf,2cfc79d9582e9135c0a9b61fa60e6b21,2018-02-19T17:11:34.000Z,40731,salvador,BA
0058f300f57d7b93c477a131a59b36c3,2,8ac44e9c15d396b8c3c7cbab0fff4536,81a93b2fa39e104b865b2bc471c16008,2018-03-22T18:09:41.000Z,41370,salvador,BA
012452d40dafae4df401bced74cdb490,1,e024c1515b1062b1e7e613f840c35ba3,ce2b4f2836d78829e4796213d536101e,2017-06-18T22:46:42.000Z,3984,sao paulo,SP
012452d40dafae4df401bced74cdb490,2,f8e05a045de09e7855c9df3bb8815e0e,e49d0607832db7c3b1343764225d8df6,2018-05-14T12:12:45.000Z,3220,sao paulo,SP
0178b244a5c281fb2ade54038dd4b161,1,483468a56a54dbbbf8f2b2354cc8a729,a72698cb5818851e1f19815692cf256b,2017-05-10T20:04:09.000Z,12518,guaratingueta,SP
0178b244a5c281fb2ade54038dd4b161,2,ea6ba2b2e27f7efea73bdeab7fd6e4a0,94ca38619d7e64f94facac403a99682d,2018-07-28T13:13:00.000Z,14960,novo horizonte,SP
018b5a7502c30eb5f230f1b4eb23a156,1,b98e0d5aca458a26a6ff30fee0416ca2,559e9d91731612dbcf09e8103ac2cd60,2017-05-18T00:41:32.000Z,74976,aparecida de goiania,GO
018b5a7502c30eb5f230f1b4eb23a156,2,026ca919d538ee454a6d43fc8bd01de0,633bd8dd4d19125b69aeee2526f79779,2017-08-20T18:10:06.000Z,74936,aparecida de goiania,GO


In [0]:
%sql
WITH customer_timeline AS (
    SELECT
        c.customer_unique_id,
        o.order_purchase_timestamp,
        COUNT(*) AS observation_count
    FROM dev_customer360.silver.validated_customers c
    INNER JOIN dev_customer360.silver.validated_orders o
        ON c.customer_id = o.customer_id
    GROUP BY
        c.customer_unique_id,
        o.order_purchase_timestamp
)

SELECT
    COUNT(*) AS tied_timestamp_groups,
    COALESCE(SUM(observation_count - 1), 0) AS additional_tied_observations,
    MAX(observation_count) AS max_observations_at_same_timestamp
FROM customer_timeline
WHERE observation_count > 1;

tied_timestamp_groups,additional_tied_observations,max_observations_at_same_timestamp
290,292,3


In [0]:
%sql
WITH customer_timeline AS (
    SELECT
        c.customer_unique_id,
        c.customer_id,
        c.customer_zip_code_prefix,
        c.customer_city,
        c.customer_state,
        o.order_purchase_timestamp,
        LAG(c.customer_zip_code_prefix) OVER (
            PARTITION BY c.customer_unique_id
            ORDER BY o.order_purchase_timestamp, c.customer_id
        ) AS previous_zip,
        LAG(c.customer_city) OVER (
            PARTITION BY c.customer_unique_id
            ORDER BY o.order_purchase_timestamp, c.customer_id
        ) AS previous_city,
        LAG(c.customer_state) OVER (
            PARTITION BY c.customer_unique_id
            ORDER BY o.order_purchase_timestamp, c.customer_id
        ) AS previous_state
    FROM dev_customer360.silver.validated_customers c
    INNER JOIN dev_customer360.silver.validated_orders o
        ON c.customer_id = o.customer_id
),
classified AS (
    SELECT
        *,
        CASE
            WHEN previous_zip IS NULL THEN 'INITIAL'
            WHEN customer_zip_code_prefix <> previous_zip
              OR customer_city <> previous_city
              OR customer_state <> previous_state
                THEN 'CHANGED'
            ELSE 'UNCHANGED'
        END AS observation_type
    FROM customer_timeline
)
SELECT
    observation_type,
    COUNT(*) AS observation_count
FROM classified
GROUP BY observation_type
ORDER BY observation_type;

observation_type,observation_count
CHANGED,259
INITIAL,96096
UNCHANGED,3086


In [0]:
%sql
WITH customer_timeline AS (
    SELECT
        c.customer_unique_id,
        c.customer_id,
        c.customer_zip_code_prefix,
        c.customer_city,
        c.customer_state,
        o.order_purchase_timestamp,
        ROW_NUMBER() OVER (
            PARTITION BY c.customer_unique_id
            ORDER BY
                o.order_purchase_timestamp,
                c.customer_id
        ) AS observation_sequence,
        LAG(c.customer_zip_code_prefix) OVER (
            PARTITION BY c.customer_unique_id
            ORDER BY
                o.order_purchase_timestamp,
                c.customer_id
        ) AS previous_zip,
        LAG(c.customer_city) OVER (
            PARTITION BY c.customer_unique_id
            ORDER BY
                o.order_purchase_timestamp,
                c.customer_id
        ) AS previous_city,
        LAG(c.customer_state) OVER (
            PARTITION BY c.customer_unique_id
            ORDER BY
                o.order_purchase_timestamp,
                c.customer_id
        ) AS previous_state
    FROM dev_customer360.silver.validated_customers c
    INNER JOIN dev_customer360.silver.validated_orders o
        ON c.customer_id = o.customer_id
),
classified AS (
    SELECT
        *,
        CASE
            WHEN observation_sequence = 1
                THEN 'INSERT'
            WHEN customer_zip_code_prefix <> previous_zip
              OR customer_city <> previous_city
              OR customer_state <> previous_state
                THEN 'UPDATE'
            ELSE 'NO_CHANGE'
        END AS event_type
    FROM customer_timeline
)
SELECT
    event_type,
    COUNT(*) AS event_count,
    COUNT(DISTINCT customer_unique_id) AS affected_customers
FROM classified
GROUP BY event_type
ORDER BY event_type;

event_type,event_count,affected_customers
INSERT,96096,96096
NO_CHANGE,3086,2767
UPDATE,259,252


In [0]:
from framework.cdc_event_generator import CDCEventGenerator
from config.cdc_config import CUSTOMER_CDC_CONFIG

In [0]:
customer_observations_df = spark.sql("""
    SELECT
        c.customer_unique_id,
        c.customer_id,
        c.customer_zip_code_prefix,
        c.customer_city,
        c.customer_state,
        o.order_id,
        o.order_purchase_timestamp
    FROM dev_customer360.silver.validated_customers c
    INNER JOIN dev_customer360.silver.validated_orders o
        ON c.customer_id = o.customer_id
""")

In [0]:
generator = CDCEventGenerator()

customer_cdc_df = generator.generate(
    customer_observations_df,
    CUSTOMER_CDC_CONFIG
)

In [0]:
display(
    customer_cdc_df
        .groupBy("_operation")
        .count()
        .orderBy("_operation")
)

_operation,count
INSERT,96096
UPDATE,259


In [0]:
from pyspark.sql.functions import col, count, countDistinct, max as spark_max

total_events = customer_cdc_df.count()
unique_change_ids = (
    customer_cdc_df
        .select("_change_id")
        .distinct()
        .count()
)
null_change_ids = (
    customer_cdc_df
        .filter(col("_change_id").isNull())
        .count()
)
null_event_timestamps = (
    customer_cdc_df
        .filter(col("_event_timestamp").isNull())
        .count()
)
duplicate_sequence_keys = (
    customer_cdc_df
        .groupBy(
            "customer_unique_id",
            "_sequence_number"
        )
        .count()
        .filter(col("count") > 1)
        .count()
)

print(f"Total CDC events              : {total_events}")
print(f"Unique change IDs             : {unique_change_ids}")
print(f"Null change IDs               : {null_change_ids}")
print(f"Null event timestamps         : {null_event_timestamps}")
print(f"Duplicate customer+sequence   : {duplicate_sequence_keys}")

Total CDC events              : 96355
Unique change IDs             : 96355
Null change IDs               : 0
Null event timestamps         : 0
Duplicate customer+sequence   : 0


In [0]:
%sql
SELECT
    _operation,
    COUNT(*) AS event_count,
    COUNT(DISTINCT _change_id) AS unique_change_ids,
    COUNT(DISTINCT customer_unique_id) AS affected_customers
FROM dev_customer360.bronze.bronze_customer_cdc
GROUP BY _operation
ORDER BY _operation;

_operation,event_count,unique_change_ids,affected_customers
INSERT,96096,96096,96096
UPDATE,259,259,252


In [0]:
%sql
SELECT
    _operation,
    MIN(_sequence_number) AS min_sequence,
    MAX(_sequence_number) AS max_sequence,
    COUNT(DISTINCT _sequence_number) AS distinct_sequences
FROM dev_customer360.bronze.bronze_customer_cdc
GROUP BY _operation
ORDER BY _operation;

_operation,min_sequence,max_sequence,distinct_sequences
INSERT,1,1,1
UPDATE,2,6,5


In [0]:
%sql
SELECT
    COUNT(*) AS duplicate_sequence_groups
FROM (
    SELECT
        customer_unique_id,
        _sequence_number,
        COUNT(*) AS event_count
    FROM dev_customer360.bronze.bronze_customer_cdc
    GROUP BY
        customer_unique_id,
        _sequence_number

    HAVING COUNT(*) > 1
);

duplicate_sequence_groups
0


In [0]:
%sql
SELECT
    COUNT(*) AS total_current_rows,
    COUNT(DISTINCT customer_unique_id) AS unique_customers,
    COUNT_IF(customer_unique_id IS NULL) AS null_customer_keys
FROM dev_customer360.silver.customer_current;

total_current_rows,unique_customers,null_customer_keys
96096,96096,0


In [0]:
%sql
SELECT
    customer_unique_id,
    customer_id,
    customer_zip_code_prefix,
    customer_city,
    customer_state,
    order_purchase_timestamp,
    _event_timestamp,
    _change_id
FROM dev_customer360.silver.customer_current
WHERE customer_unique_id =
      '0178b244a5c281fb2ade54038dd4b161';

customer_unique_id,customer_id,customer_zip_code_prefix,customer_city,customer_state,order_purchase_timestamp,_event_timestamp,_change_id
0178b244a5c281fb2ade54038dd4b161,ea6ba2b2e27f7efea73bdeab7fd6e4a0,14960,novo horizonte,SP,2018-07-28T13:13:00.000Z,2018-07-28T13:13:00.000Z,45c0ac19ac6f02c8b61b23d6844a72f7f19b2267b829781e5e4c954af1df83d9


In [0]:
%sql
SELECT
    COUNT(*) AS total_history_rows,
    COUNT(DISTINCT customer_unique_id) AS unique_customers,
    COUNT_IF(customer_unique_id IS NULL) AS null_customer_keys
FROM dev_customer360.silver.customer_history;

total_history_rows,unique_customers,null_customer_keys
96355,96096,0


In [0]:
%sql
SELECT *
FROM dev_customer360.silver.customer_history
WHERE customer_unique_id =
      '0178b244a5c281fb2ade54038dd4b161'
ORDER BY __START_AT;

customer_unique_id,customer_id,customer_zip_code_prefix,customer_city,customer_state,order_id,order_purchase_timestamp,_event_timestamp,_change_id,__START_AT,__END_AT
0178b244a5c281fb2ade54038dd4b161,483468a56a54dbbbf8f2b2354cc8a729,12518,guaratingueta,SP,a72698cb5818851e1f19815692cf256b,2017-05-10T20:04:09.000Z,2017-05-10T20:04:09.000Z,9fbe63a026ccab2eb1a90b5774fd7738b9130c6a76bb095ecfd46b1de7dda0f1,1,2
0178b244a5c281fb2ade54038dd4b161,ea6ba2b2e27f7efea73bdeab7fd6e4a0,14960,novo horizonte,SP,94ca38619d7e64f94facac403a99682d,2018-07-28T13:13:00.000Z,2018-07-28T13:13:00.000Z,45c0ac19ac6f02c8b61b23d6844a72f7f19b2267b829781e5e4c954af1df83d9,2,null


In [0]:
%sql
DESCRIBE DETAIL dev_customer360.silver.customer_current;

format,id,name,description,location,createdAt,lastModified,partitionColumns,clusteringColumns,numFiles,sizeInBytes,properties,minReaderVersion,minWriterVersion,tableFeatures,statistics,clusterByAuto
delta,29b9d4e8-bb23-4065-b435-1477a2982bdf,dev_customer360.silver.__materialization_mat_c96b08f5_0807_4432_8121_ab86f444344f_customer_current_1,Current customer profile maintained using Lakeflow AUTO CDC with SCD Type 1 semantics.,s3://dbstorage-prod-lbwhs/uc/4655a398-48b7-4b56-bd8e-44f51360a1af/17026741-d5eb-47e8-ad20-e9b45978fd3b/__unitystorage/catalogs/b3fd5571-a6fe-49ff-adb9-b3bf1730929e/tables/1a0a921f-ac3f-49b3-96fb-63df1167e917,2026-10-04T12:30:29.117Z,2026-10-04T12:31:33.000Z,List(),List(),1,10018417,"Map(pipelines.autoCdc.version -> v2, delta.parquet.compression.codec -> zstd, spark.internal.pipelines.reconciliation_query_without_timetravel -> SELECT * EXCEPT (`__Timestamp`, `__DeleteVersion`, `__UpsertVersion`, `__DROP_EXPECTATIONS_COL`, `__MEETS_DROP_EXPECTATIONS`, `__ALLOW_EXPECTATIONS_COL`) FROM `dev_customer360`.`silver`.`__materialization_mat_c96b08f5_0807_4432_8121_ab86f444344f_customer_current_1`WHERE __DeleteVersion IS NULL AND (__MEETS_DROP_EXPECTATIONS IS NULL or __MEETS_DROP_EXPECTATIONS), pipeline_internal.catalogType -> UNITY_CATALOG, delta.enableChangeDataFeed -> true, spark.sql.internal.pipelines.parentTableId -> 3672b9cb-b5d1-4737-a6a2-6afecd0df4ef, delta.enableDeletionVectors -> true, pipelines.pipelineId -> c96b08f5-0807-4432-8121-ab86f444344f, pipeline_internal.enzymeMode -> Advanced, spark.internal.streaming_table.parentTable -> `dev_customer360`.`silver`.`customer_current`, delta.enableRowTracking -> true, io.unitycatalog.tableId -> 1a0a921f-ac3f-49b3-96fb-63df1167e917, delta.rowTracking.materializedRowCommitVersionColumnName -> _row-commit-version-col-4c21744a-5e4d-41cd-a5d2-014524505ebc, pipelines.metastore.tableName -> `dev_customer360`.`silver`.`customer_current`, delta.rowTracking.materializedRowIdColumnName -> _row-id-col-7a642604-cae7-4627-a973-47c295f5ae53)",3,7,"List(appendOnly, changeDataFeed, deletionVectors, domainMetadata, invariants, rowTracking)","Map(numRowsDeletedByDeletionVectors -> 0, numDeletionVectors -> 0)",false


In [0]:
%sql
DESCRIBE DETAIL dev_customer360.silver.customer_history;

format,id,name,description,location,createdAt,lastModified,partitionColumns,clusteringColumns,numFiles,sizeInBytes,properties,minReaderVersion,minWriterVersion,tableFeatures,statistics,clusterByAuto
delta,65e88b74-341d-4c47-a56a-3e3ab5428c31,dev_customer360.silver.__materialization_mat_c96b08f5_0807_4432_8121_ab86f444344f_customer_history_1,Historical customer profile maintained using Lakeflow AUTO CDC with SCD Type 2 semantics.,s3://dbstorage-prod-lbwhs/uc/4655a398-48b7-4b56-bd8e-44f51360a1af/17026741-d5eb-47e8-ad20-e9b45978fd3b/__unitystorage/catalogs/b3fd5571-a6fe-49ff-adb9-b3bf1730929e/tables/b87b98bb-e660-4b8a-acd6-f420bde9a694,2026-10-04T12:48:19.765Z,2026-10-04T12:49:06.000Z,List(),List(),1,10045961,"Map(pipelines.autoCdc.version -> v2, delta.parquet.compression.codec -> zstd, spark.internal.pipelines.reconciliation_query_without_timetravel -> SELECT * EXCEPT (`__recordStartAt`, `__rowIsHidden`, `__DROP_EXPECTATIONS_COL`, `__MEETS_DROP_EXPECTATIONS`, `__ALLOW_EXPECTATIONS_COL`) FROM `dev_customer360`.`silver`.`__materialization_mat_c96b08f5_0807_4432_8121_ab86f444344f_customer_history_1`WHERE (__rowIsHidden IS NULL or NOT __rowIsHidden) AND (__MEETS_DROP_EXPECTATIONS IS NULL or __MEETS_DROP_EXPECTATIONS), pipeline_internal.catalogType -> UNITY_CATALOG, delta.enableChangeDataFeed -> true, spark.sql.internal.pipelines.parentTableId -> 5b6b8773-17cf-4d03-8867-36713b525e4b, delta.enableDeletionVectors -> true, pipelines.pipelineId -> c96b08f5-0807-4432-8121-ab86f444344f, pipeline_internal.enzymeMode -> Advanced, spark.internal.streaming_table.parentTable -> `dev_customer360`.`silver`.`customer_history`, delta.enableRowTracking -> true, io.unitycatalog.tableId -> b87b98bb-e660-4b8a-acd6-f420bde9a694, delta.rowTracking.materializedRowCommitVersionColumnName -> _row-commit-version-col-8cc7f6d3-0061-4acb-bd8b-bda8c9029fa6, pipelines.metastore.tableName -> `dev_customer360`.`silver`.`customer_history`, delta.rowTracking.materializedRowIdColumnName -> _row-id-col-1c7bf4a1-d499-40f9-9b9c-0ec32bff1b20)",3,7,"List(appendOnly, changeDataFeed, deletionVectors, domainMetadata, invariants, rowTracking)","Map(numRowsDeletedByDeletionVectors -> 0, numDeletionVectors -> 0)",false


In [0]:
%sql
SELECT
    order_status,
    COUNT(*) AS total_orders,
    COUNT(order_purchase_timestamp) AS has_purchase_timestamp,
    COUNT(order_approved_at) AS has_approval_timestamp,
    COUNT(order_delivered_carrier_date) AS has_carrier_timestamp,
    COUNT(order_delivered_customer_date) AS has_delivery_timestamp,
    COUNT(order_estimated_delivery_date) AS has_estimated_delivery_date
FROM dev_customer360.silver.validated_orders
GROUP BY order_status
ORDER BY total_orders DESC;

order_status,total_orders,has_purchase_timestamp,has_approval_timestamp,has_carrier_timestamp,has_delivery_timestamp,has_estimated_delivery_date
delivered,96478,96478,96464,96476,96470,96478
shipped,1107,1107,1107,1107,0,1107
canceled,625,625,484,75,6,625
unavailable,609,609,609,0,0,609
invoiced,314,314,314,0,0,314
processing,301,301,301,0,0,301
created,5,5,0,0,0,5
approved,2,2,2,0,0,2


In [0]:
%sql
SELECT
    order_status,
    COUNT(*) AS total_orders,
    COUNT_IF(
        order_approved_at IS NOT NULL
    ) AS approved_stage_reached,
    COUNT_IF(
        order_delivered_carrier_date IS NOT NULL
    ) AS carrier_stage_reached,
    COUNT_IF(
        order_delivered_customer_date IS NOT NULL
    ) AS delivery_stage_reached,
    COUNT_IF(
        order_delivered_customer_date IS NOT NULL
        AND order_status <> 'delivered'
    ) AS delivered_timestamp_but_not_delivered_status,
    COUNT_IF(
        order_status = 'delivered'
        AND order_delivered_customer_date IS NULL
    ) AS delivered_status_without_delivery_timestamp
FROM dev_customer360.silver.validated_orders
GROUP BY order_status
ORDER BY total_orders DESC;

order_status,total_orders,approved_stage_reached,carrier_stage_reached,delivery_stage_reached,delivered_timestamp_but_not_delivered_status,delivered_status_without_delivery_timestamp
delivered,96478,96464,96476,96470,0,8
shipped,1107,1107,1107,0,0,0
canceled,625,484,75,6,6,0
unavailable,609,609,0,0,0,0
invoiced,314,314,0,0,0,0
processing,301,301,0,0,0,0
created,5,0,0,0,0,0
approved,2,2,0,0,0,0


In [0]:
%sql
SELECT
    order_status,
    COUNT(*) AS total_orders,
    MIN(order_purchase_timestamp) AS min_purchase,
    MAX(order_purchase_timestamp) AS max_purchase,
    COUNT_IF(order_approved_at IS NULL)
        AS missing_approval,
    COUNT_IF(order_delivered_carrier_date IS NULL)
        AS missing_carrier,
    COUNT_IF(order_delivered_customer_date IS NULL)
        AS missing_delivery,
    COUNT_IF(
        order_delivered_carrier_date IS NOT NULL
        AND order_delivered_carrier_date < order_approved_at
    ) AS carrier_before_approval,
    COUNT_IF(
        order_delivered_customer_date IS NOT NULL
        AND order_delivered_carrier_date IS NOT NULL
        AND order_delivered_customer_date < order_delivered_carrier_date
    ) AS delivery_before_carrier
FROM dev_customer360.silver.validated_orders
WHERE order_status IN ('canceled', 'unavailable')
GROUP BY order_status
ORDER BY order_status;

order_status,total_orders,min_purchase,max_purchase,missing_approval,missing_carrier,missing_delivery,carrier_before_approval,delivery_before_carrier
canceled,625,2016-09-05T00:15:34.000Z,2018-10-17T17:30:18.000Z,141,550,619,0,0
unavailable,609,2016-10-05T14:16:28.000Z,2018-08-21T12:21:00.000Z,0,609,609,0,0


In [0]:
%sql
SELECT
    order_id,
    customer_id,
    order_status,
    order_purchase_timestamp,
    order_approved_at,
    order_delivered_carrier_date,
    order_delivered_customer_date,
    order_estimated_delivery_date
FROM dev_customer360.silver.validated_orders
WHERE order_status = 'delivered'
  AND order_delivered_customer_date IS NULL
ORDER BY order_purchase_timestamp;

order_id,customer_id,order_status,order_purchase_timestamp,order_approved_at,order_delivered_carrier_date,order_delivered_customer_date,order_estimated_delivery_date
2d858f451373b04fb5c984a1cc2defaf,e08caf668d499a6d643dafd7c5cc498a,delivered,2017-05-25T23:22:43.000Z,2017-05-25T23:30:16.000Z,null,null,2017-06-23T00:00:00.000Z
2d1e2d5bf4dc7227b3bfebb81328c15f,ec05a6d8558c6455f0cbbd8a420ad34f,delivered,2017-11-28T17:44:07.000Z,2017-11-28T17:56:40.000Z,2017-11-30T18:12:23.000Z,null,2017-12-18T00:00:00.000Z
ab7c89dc1bf4a1ead9d6ec1ec8968a84,dd1b84a7286eb4524d52af4256c0ba24,delivered,2018-06-08T12:09:39.000Z,2018-06-08T12:36:39.000Z,2018-06-12T14:10:00.000Z,null,2018-06-26T00:00:00.000Z
f5dd62b788049ad9fc0526e3ad11a097,5e89028e024b381dc84a13a3570decb4,delivered,2018-06-20T06:58:43.000Z,2018-06-20T07:19:05.000Z,2018-06-25T08:05:00.000Z,null,2018-07-16T00:00:00.000Z
20edc82cf5400ce95e1afacc25798b31,28c37425f1127d887d7337f284080a0f,delivered,2018-06-27T16:09:12.000Z,2018-06-27T16:29:30.000Z,2018-07-03T19:26:00.000Z,null,2018-07-19T00:00:00.000Z
2ebdfc4f15f23b91474edf87475f108e,29f0540231702fda0cfdee0a310f11aa,delivered,2018-07-01T17:05:11.000Z,2018-07-01T17:15:12.000Z,2018-07-03T13:57:00.000Z,null,2018-07-30T00:00:00.000Z
0d3268bad9b086af767785e3f0fc0133,4f1d63d35fb7c8999853b2699f5c7649,delivered,2018-07-01T21:14:02.000Z,2018-07-01T21:29:54.000Z,2018-07-03T09:28:00.000Z,null,2018-07-24T00:00:00.000Z
e69f75a717d64fc5ecdfae42b2e8e086,cfda40ca8dd0a5d486a9635b611b398a,delivered,2018-07-01T22:05:55.000Z,2018-07-01T22:15:14.000Z,2018-07-03T13:57:00.000Z,null,2018-07-30T00:00:00.000Z


In [0]:
from config.order_lifecycle_config import ORDER_LIFECYCLE_EVENTS

for event in ORDER_LIFECYCLE_EVENTS:
    print(
        event.event_type,
        "->",
        event.timestamp_column,
        "->",
        event.resulting_status
    )

PURCHASED -> order_purchase_timestamp -> purchased
APPROVED -> order_approved_at -> approved
SHIPPED -> order_delivered_carrier_date -> shipped
DELIVERED -> order_delivered_customer_date -> delivered


In [0]:
%sql
SELECT
    COUNT_IF(
        order_purchase_timestamp = order_approved_at
    ) AS purchase_equals_approval,

    COUNT_IF(
        order_approved_at = order_delivered_carrier_date
    ) AS approval_equals_carrier,

    COUNT_IF(
        order_delivered_carrier_date = order_delivered_customer_date
    ) AS carrier_equals_delivery,

    COUNT_IF(
        order_purchase_timestamp = order_delivered_carrier_date
    ) AS purchase_equals_carrier,

    COUNT_IF(
        order_purchase_timestamp = order_delivered_customer_date
    ) AS purchase_equals_delivery,

    COUNT_IF(
        order_approved_at = order_delivered_customer_date
    ) AS approval_equals_delivery

FROM dev_customer360.silver.validated_orders;

purchase_equals_approval,approval_equals_carrier,carrier_equals_delivery,purchase_equals_carrier,purchase_equals_delivery,approval_equals_delivery
1296,0,9,0,0,0


In [0]:
from framework.order_lifecycle_event_generator import (
    OrderLifecycleEventGenerator
)

orders_df = spark.table(
    "dev_customer360.silver.validated_orders"
)

generator = OrderLifecycleEventGenerator()

order_cdc_df = generator.generate(orders_df)

display(
    order_cdc_df
    .groupBy("_event_type", "_operation")
    .count()
    .orderBy("_event_type")
)

_event_type,_operation,count
APPROVED,UPDATE,99281
DELIVERED,UPDATE,96476
PURCHASED,INSERT,99441
SHIPPED,UPDATE,97492


In [0]:
%sql
SELECT
    COUNT(*) AS carrier_before_purchase_count,

    MIN(
        unix_timestamp(order_purchase_timestamp)
        - unix_timestamp(order_delivered_carrier_date)
    ) AS min_difference_seconds,

    MAX(
        unix_timestamp(order_purchase_timestamp)
        - unix_timestamp(order_delivered_carrier_date)
    ) AS max_difference_seconds

FROM dev_customer360.silver.validated_orders

WHERE order_delivered_carrier_date IS NOT NULL
  AND order_delivered_carrier_date < order_purchase_timestamp;

carrier_before_purchase_count,min_difference_seconds,max_difference_seconds
166,24,14792753


In [0]:
%sql
SELECT
    order_id,
    order_status,
    order_purchase_timestamp,
    order_approved_at,
    order_delivered_carrier_date,
    order_delivered_customer_date

FROM dev_customer360.silver.validated_orders

WHERE order_delivered_carrier_date IS NOT NULL
  AND order_delivered_carrier_date < order_purchase_timestamp

ORDER BY order_purchase_timestamp

LIMIT 10;

order_id,order_status,order_purchase_timestamp,order_approved_at,order_delivered_carrier_date,order_delivered_customer_date
fd58bdbb6cc5d7519e063c3ceb7e951b,delivered,2018-04-25T13:02:26.000Z,2018-04-25T13:15:26.000Z,2018-04-25T12:36:00.000Z,2018-05-08T16:32:17.000Z
b4180badf3ac49892e23d6e0276f1e84,delivered,2018-04-26T14:44:05.000Z,2018-04-26T14:55:14.000Z,2018-04-26T13:51:00.000Z,2018-05-03T00:14:44.000Z
e4c540c341b9a50b1a1b28e71867eb5b,delivered,2018-04-26T15:55:42.000Z,2018-04-26T16:11:01.000Z,2018-04-26T14:55:00.000Z,2018-04-27T17:24:52.000Z
9e6928e55ec6948338048d72ebdf2305,delivered,2018-04-27T15:12:36.000Z,2018-04-27T15:32:59.000Z,2018-04-27T15:08:00.000Z,2018-05-07T19:03:52.000Z
5a339130640419f9e00ab4b6ff61dc22,delivered,2018-04-27T15:59:23.000Z,2018-04-27T16:15:25.000Z,2018-04-27T14:35:00.000Z,2018-05-02T15:32:39.000Z
55b653f93de6e994b6dda90f615c7a8f,delivered,2018-04-30T13:05:23.000Z,2018-04-30T13:15:21.000Z,2018-04-30T13:01:00.000Z,2018-05-04T18:03:43.000Z
dee6298ce7d1fb2645141ef9972157aa,shipped,2018-04-30T14:06:12.000Z,2018-04-30T14:15:24.000Z,2018-04-30T12:59:00.000Z,null
51e0e77bc0b6eb43fc25286a873ceac6,delivered,2018-04-30T14:55:34.000Z,2018-04-30T16:17:13.000Z,2018-04-30T14:41:00.000Z,2018-05-07T16:08:49.000Z
74e033208dc13a7b8127eb8e73d09b76,delivered,2018-05-02T10:48:44.000Z,2018-05-02T11:13:45.000Z,2018-05-02T09:49:00.000Z,2018-05-07T23:06:36.000Z
2e404f3ac4dd39d7054b4cbb88ce2c35,delivered,2018-05-04T09:49:02.000Z,2018-05-04T10:11:27.000Z,2018-05-04T09:41:00.000Z,2018-05-09T12:08:37.000Z


In [0]:
import importlib
import framework.order_lifecycle_event_generator as order_generator_module

importlib.reload(order_generator_module)

OrderLifecycleEventGenerator = (
    order_generator_module.OrderLifecycleEventGenerator
)

generator = OrderLifecycleEventGenerator()

orders_df = spark.table(
    "dev_customer360.silver.validated_orders"
)

order_cdc_df = generator.generate(orders_df)

display(
    order_cdc_df
    .groupBy("_event_type", "_operation")
    .count()
    .orderBy("_event_type", "_operation")
)

_event_type,_operation,count
APPROVED,UPDATE,99281
DELIVERED,UPDATE,96476
PURCHASED,INSERT,99441
SHIPPED,UPDATE,97492


In [0]:
from pyspark.sql.functions import col

display(
    order_cdc_df
    .filter(
        (col("_event_type") == "SHIPPED")
        & (
            col("_event_timestamp")
            < col("order_purchase_timestamp")
        )
    )
    .select(
        "order_id",
        "_event_type",
        "_event_timestamp",
        "order_purchase_timestamp",
        "_sequence_number",
        "_operation"
    )
)

order_id,_event_type,_event_timestamp,order_purchase_timestamp,_sequence_number,_operation


In [0]:
bad_shipped_count = (
    order_cdc_df
    .filter(
        (col("_event_type") == "SHIPPED")
        & (
            col("_event_timestamp")
            < col("order_purchase_timestamp")
        )
    )
    .count()
)

print("Invalid SHIPPED CDC events:", bad_shipped_count)

Invalid SHIPPED CDC events: 0


In [0]:
from pyspark.sql.functions import col, count, countDistinct

summary = (
    order_cdc_df
    .agg(
        count("*").alias("total_cdc_events"),
        countDistinct("_change_id").alias("unique_change_ids"),
        countDistinct("order_id").alias("orders_in_cdc")
    )
)

display(summary)

total_cdc_events,unique_change_ids,orders_in_cdc
392690,392690,99441


In [0]:
display(
    order_cdc_df
    .groupBy("_event_type")
    .agg(
        count("*").alias("event_count"),
        countDistinct("order_id").alias("affected_orders")
    )
    .orderBy("_event_type")
)

_event_type,event_count,affected_orders
APPROVED,99281,99281
DELIVERED,96476,96476
PURCHASED,99441,99441
SHIPPED,97492,97492


In [0]:
from pyspark.sql.functions import col

source_carrier_total = (
    orders_df
    .filter(
        col("order_delivered_carrier_date").isNotNull()
    )
    .count()
)

source_valid_carrier = (
    orders_df
    .filter(
        col("order_delivered_carrier_date").isNotNull()
        & (
            col("order_delivered_carrier_date")
            >= col("order_purchase_timestamp")
        )
    )
    .count()
)

source_invalid_carrier = (
    orders_df
    .filter(
        col("order_delivered_carrier_date").isNotNull()
        & (
            col("order_delivered_carrier_date")
            < col("order_purchase_timestamp")
        )
    )
    .count()
)

generated_shipped = (
    order_cdc_df
    .filter(col("_event_type") == "SHIPPED")
    .count()
)

print("Source carrier total :", source_carrier_total)
print("Source valid carrier :", source_valid_carrier)
print("Source invalid carrier:", source_invalid_carrier)
print("Generated SHIPPED    :", generated_shipped)

Source carrier total : 97658
Source valid carrier : 97492
Source invalid carrier: 166
Generated SHIPPED    : 97492


In [0]:
from pyspark.sql.functions import (
    col,
    count,
    countDistinct,
    min,
    max
)

display(
    order_cdc_df
    .groupBy("_event_type")
    .agg(
        count("*").alias("event_count"),
        min("_sequence_number").alias("min_sequence"),
        max("_sequence_number").alias("max_sequence"),
        countDistinct("_sequence_number").alias(
            "distinct_sequences"
        )
    )
    .orderBy("_event_type")
)

_event_type,event_count,min_sequence,max_sequence,distinct_sequences
APPROVED,99281,2,4,3
DELIVERED,96476,3,4,2
PURCHASED,99441,1,1,1
SHIPPED,97492,2,4,3


In [0]:
duplicate_sequences = (
    order_cdc_df
    .groupBy(
        "order_id",
        "_sequence_number"
    )
    .count()
    .filter(col("count") > 1)
    .count()
)

print(
    "Duplicate order + sequence groups:",
    duplicate_sequences
)

Duplicate order + sequence groups: 0


In [0]:
%sql
SELECT
    _event_type,
    _operation,
    COUNT(*) AS event_count,
    COUNT(DISTINCT order_id) AS affected_orders,
    COUNT(DISTINCT _change_id) AS unique_change_ids
FROM dev_customer360.bronze.bronze_order_cdc
GROUP BY _event_type, _operation
ORDER BY _event_type, _operation;

_event_type,_operation,event_count,affected_orders,unique_change_ids
APPROVED,UPDATE,99281,99281,99281
DELIVERED,UPDATE,96476,96476,96476
PURCHASED,INSERT,99441,99441,99441
SHIPPED,UPDATE,97492,97492,97492


In [0]:
%sql
SELECT
    COUNT(*) AS total_cdc_events,
    COUNT(DISTINCT order_id) AS distinct_orders,
    COUNT(DISTINCT _change_id) AS unique_change_ids,
    COUNT_IF(_change_id IS NULL) AS null_change_ids,
    COUNT_IF(_event_timestamp IS NULL) AS null_event_timestamps
FROM dev_customer360.bronze.bronze_order_cdc;

total_cdc_events,distinct_orders,unique_change_ids,null_change_ids,null_event_timestamps
392690,99441,392690,0,0


In [0]:
%sql
SELECT
    COUNT(*) AS total_current_rows,
    COUNT(DISTINCT order_id) AS unique_orders,
    COUNT_IF(order_id IS NULL) AS null_order_ids,
    COUNT_IF(_change_id IS NULL) AS null_change_ids
FROM dev_customer360.silver.order_current;

total_current_rows,unique_orders,null_order_ids,null_change_ids
99441,99441,0,0


In [0]:
%sql
SELECT
    order_status,
    COUNT(*) AS order_count
FROM dev_customer360.silver.order_current
GROUP BY order_status
ORDER BY order_count DESC;

order_status,order_count
delivered,96392
approved,1706
shipped,1197
purchased,146


In [0]:
%sql
SELECT
    src.order_status AS source_final_status,
    cur.order_status AS reconstructed_current_status,
    COUNT(*) AS order_count

FROM dev_customer360.silver.validated_orders src

JOIN dev_customer360.silver.order_current cur
    ON src.order_id = cur.order_id

GROUP BY
    src.order_status,
    cur.order_status

ORDER BY
    source_final_status,
    order_count DESC;

source_final_status,reconstructed_current_status,order_count
approved,approved,2
canceled,approved,409
canceled,purchased,141
canceled,shipped,69
canceled,delivered,6
created,purchased,5
delivered,delivered,96386
delivered,approved,62
delivered,shipped,30
invoiced,approved,314


In [0]:
%sql
SELECT
    COUNT(*) AS total_history_rows,
    COUNT(DISTINCT order_id) AS unique_orders,
    COUNT_IF(order_id IS NULL) AS null_order_ids,
    COUNT_IF(_change_id IS NULL) AS null_change_ids
FROM dev_customer360.silver.order_history;

total_history_rows,unique_orders,null_order_ids,null_change_ids
392690,99441,0,0


In [0]:
%sql
SELECT
    COUNT_IF(__END_AT IS NULL) AS current_versions,
    COUNT_IF(__END_AT IS NOT NULL) AS historical_versions,
    COUNT(*) AS total_versions
FROM dev_customer360.silver.order_history;

current_versions,historical_versions,total_versions
99441,293249,392690


In [0]:
simulator_base_path = (
    "/Volumes/dev_customer360/bronze/landing/cdc_simulator"
)

customer_simulator_path = (
    f"{simulator_base_path}/customers"
)

order_simulator_path = (
    f"{simulator_base_path}/orders"
)

dbutils.fs.mkdirs(customer_simulator_path)
dbutils.fs.mkdirs(order_simulator_path)

print("Customer CDC simulator:")
print(customer_simulator_path)

print("\nOrder CDC simulator:")
print(order_simulator_path)

Customer CDC simulator:
/Volumes/dev_customer360/bronze/landing/cdc_simulator/customers

Order CDC simulator:
/Volumes/dev_customer360/bronze/landing/cdc_simulator/orders


In [0]:
%sql
SELECT
    MAX(_sequence_number) AS max_baseline_sequence,
    COUNT(DISTINCT customer_unique_id) AS customers
FROM dev_customer360.bronze.bronze_customer_cdc;

max_baseline_sequence,customers
6,96096


In [0]:
%sql
SELECT
    customer_unique_id,
    MAX(_sequence_number) AS latest_sequence
FROM dev_customer360.bronze.bronze_customer_cdc
GROUP BY customer_unique_id
ORDER BY latest_sequence DESC
LIMIT 10;

customer_unique_id,latest_sequence
3e43e6105506432c953e165fb2acf44c,6
47c1a3033b8b77b3ab6e109eb4d5fdf3,4
f34cd7fd85a1f8baff886edf09567be3,4
e325e139452a1ca05f5a33acedd7d94f,3
b9badb100ff8ecc16a403111209e3a06,3
c2919fbdb45366551c1e80d5cb35cd3f,3
4e1cce07cd5937c69dacac3c8b13d965,3
738ffcf1017b584e9d2684b36e07469c,3
bf6656ef50e6fd00e7517b01d615b4f3,3
fe59d5878cd80080edbd29b5a0a4e1cf,3


In [0]:
%sql
SELECT
    cur.customer_unique_id,
    cur.customer_id,
    cur.customer_zip_code_prefix,
    cur.customer_city,
    cur.customer_state,
    cur._event_timestamp,
    MAX(cdc._sequence_number) AS latest_sequence

FROM dev_customer360.silver.customer_current cur

JOIN dev_customer360.bronze.bronze_customer_cdc cdc
    ON cur.customer_unique_id = cdc.customer_unique_id

GROUP BY
    cur.customer_unique_id,
    cur.customer_id,
    cur.customer_zip_code_prefix,
    cur.customer_city,
    cur.customer_state,
    cur._event_timestamp

HAVING MAX(cdc._sequence_number) = 1

ORDER BY cur.customer_unique_id

LIMIT 1;

customer_unique_id,customer_id,customer_zip_code_prefix,customer_city,customer_state,_event_timestamp,latest_sequence
0000366f3b9a7992bf8c76cfdf3221e2,fadbb3709178fc513abc1b2670aa1ad2,7787,cajamar,SP,2018-05-10T10:56:27.000Z,1


In [0]:
from config.schemas import CUSTOMER_CDC_SIMULATOR_SCHEMA

from datetime import datetime
from pyspark.sql import Row

customer_update_event = [
    Row(
        customer_unique_id="0000366f3b9a7992bf8c76cfdf3221e2",
        customer_id="fadbb3709178fc513abc1b2670aa1ad2",

        # Simulated new profile
        customer_zip_code_prefix=80010,
        customer_city="curitiba",
        customer_state="PR",

        _operation="UPDATE",
        _event_timestamp=datetime(2026, 10, 4, 22, 0, 0),
        _sequence_number=2,
        _change_id="SIM_CUSTOMER_UPDATE_001",
    )
]

customer_update_df = spark.createDataFrame(
    customer_update_event,
    schema=CUSTOMER_CDC_SIMULATOR_SCHEMA
)

display(customer_update_df)

customer_unique_id,customer_id,customer_zip_code_prefix,customer_city,customer_state,_operation,_event_timestamp,_sequence_number,_change_id
0000366f3b9a7992bf8c76cfdf3221e2,fadbb3709178fc513abc1b2670aa1ad2,80010,curitiba,PR,UPDATE,2026-10-04T22:00:00.000Z,2,SIM_CUSTOMER_UPDATE_001


In [0]:
from datetime import datetime
from pyspark.sql import Row

customer_update_event = [
    Row(
        customer_unique_id="0000366f3b9a7992bf8c76cfdf3221e2",
        customer_id="fadbb3709178fc513abc1b2670aa1ad2",
        customer_zip_code_prefix=80010,
        customer_city="curitiba",
        customer_state="PR",
        _operation="UPDATE",
        _event_timestamp=datetime(2026, 10, 4, 22, 0, 0),
        _sequence_number=2,
        _change_id="SIM_CUSTOMER_UPDATE_001",
    )
]

customer_update_df = spark.createDataFrame(
    customer_update_event,
    schema=CUSTOMER_CDC_SIMULATOR_SCHEMA
)

display(customer_update_df)

customer_unique_id,customer_id,customer_zip_code_prefix,customer_city,customer_state,_operation,_event_timestamp,_sequence_number,_change_id
0000366f3b9a7992bf8c76cfdf3221e2,fadbb3709178fc513abc1b2670aa1ad2,80010,curitiba,PR,UPDATE,2026-10-04T22:00:00.000Z,2,SIM_CUSTOMER_UPDATE_001


In [0]:
from pyspark.sql.functions import col, count, countDistinct

validation = (
    customer_update_df
    .agg(
        count("*").alias("event_count"),
        countDistinct("_change_id").alias("unique_change_ids"),
        countDistinct("customer_unique_id").alias("customers"),
    )
)

display(validation)

event_count,unique_change_ids,customers
1,1,1


In [0]:
invalid_events = (
    customer_update_df
    .filter(
        col("customer_unique_id").isNull()
        | col("_operation").isNull()
        | (~col("_operation").isin("INSERT", "UPDATE", "DELETE"))
        | col("_event_timestamp").isNull()
        | col("_sequence_number").isNull()
        | col("_change_id").isNull()
    )
    .count()
)

print("Invalid simulator events:", invalid_events)

Invalid simulator events: 0


In [0]:
customer_simulator_path = (
    "/Volumes/dev_customer360/bronze/landing/"
    "cdc_simulator/customers"
)

(
    customer_update_df
    .coalesce(1)
    .write
    .mode("append")
    .option("header", "true")
    .csv(customer_simulator_path)
)

print("Customer CDC event landed successfully.")

Customer CDC event landed successfully.


In [0]:
display(
    dbutils.fs.ls(customer_simulator_path)
)

path,name,size,modificationTime
dbfs:/Volumes/dev_customer360/bronze/landing/cdc_simulator/customers/_SUCCESS,_SUCCESS,0,1791131292000
dbfs:/Volumes/dev_customer360/bronze/landing/cdc_simulator/customers/_committed_968174682355327624,_committed_968174682355327624,112,1791131292000
dbfs:/Volumes/dev_customer360/bronze/landing/cdc_simulator/customers/_started_968174682355327624,_started_968174682355327624,0,1791131291000
dbfs:/Volumes/dev_customer360/bronze/landing/cdc_simulator/customers/part-00000-tid-968174682355327624-56953e5f-99b1-41ed-9b6c-c6d74ddb6eb6-177-1-c000.csv,part-00000-tid-968174682355327624-56953e5f-99b1-41ed-9b6c-c6d74ddb6eb6-177-1-c000.csv,283,1791131291000


In [0]:
%sql
SELECT
    customer_unique_id,
    customer_id,
    customer_zip_code_prefix,
    customer_city,
    customer_state,
    _operation,
    _event_timestamp,
    _sequence_number,
    _change_id,
    _source_system,
    _source_entity,
    _source_file_name,
    _rescued_data
FROM dev_customer360.bronze.bronze_customer_cdc_simulated;

customer_unique_id,customer_id,customer_zip_code_prefix,customer_city,customer_state,_operation,_event_timestamp,_sequence_number,_change_id,_source_system,_source_entity,_source_file_name,_rescued_data
0000366f3b9a7992bf8c76cfdf3221e2,fadbb3709178fc513abc1b2670aa1ad2,80010,curitiba,PR,UPDATE,2026-10-04T22:00:00.000Z,2,SIM_CUSTOMER_UPDATE_001,cdc_simulator,customer_cdc_simulator,part-00000-tid-968174682355327624-56953e5f-99b1-41ed-9b6c-c6d74ddb6eb6-177-1-c000.csv,null


In [0]:
%sql
SELECT
    COUNT(*) AS total_events,
    COUNT(DISTINCT _change_id) AS unique_change_ids,
    COUNT_IF(_change_id IS NULL) AS null_change_ids,
    COUNT_IF(_event_timestamp IS NULL) AS null_event_timestamps,
    COUNT_IF(_sequence_number IS NULL) AS null_sequences,
    COUNT_IF(_rescued_data IS NOT NULL) AS rescued_events
FROM dev_customer360.bronze.bronze_customer_cdc_simulated;

total_events,unique_change_ids,null_change_ids,null_event_timestamps,null_sequences,rescued_events
1,1,0,0,0,0


In [0]:
%sql
SELECT
    customer_unique_id,
    customer_id,
    customer_zip_code_prefix,
    customer_city,
    customer_state,
    _event_timestamp,
    _change_id
FROM dev_customer360.silver.customer_current
WHERE customer_unique_id =
    '0000366f3b9a7992bf8c76cfdf3221e2';

customer_unique_id,customer_id,customer_zip_code_prefix,customer_city,customer_state,_event_timestamp,_change_id
0000366f3b9a7992bf8c76cfdf3221e2,fadbb3709178fc513abc1b2670aa1ad2,7787,cajamar,SP,2018-05-10T10:56:27.000Z,397528cb28f94ec31114308697e6c43303279aa6099a747494aafe80333fb73b


In [0]:
%sql
DESCRIBE EXTENDED dev_customer360.bronze.bronze_customer_cdc;

col_name,data_type,comment
customer_unique_id,string,null
customer_id,string,null
customer_zip_code_prefix,int,null
customer_city,string,null
customer_state,string,null
order_id,string,null
order_purchase_timestamp,timestamp,null
_sequence_number,int,null
_operation,string,null
_event_timestamp,timestamp,null


In [0]:
%sql
SELECT
    customer_unique_id,
    customer_id,
    customer_zip_code_prefix,
    customer_city,
    customer_state,
    _event_timestamp,
    _change_id
FROM dev_customer360.silver.customer_current
WHERE customer_unique_id =
    '0000366f3b9a7992bf8c76cfdf3221e2';

customer_unique_id,customer_id,customer_zip_code_prefix,customer_city,customer_state,_event_timestamp,_change_id
0000366f3b9a7992bf8c76cfdf3221e2,fadbb3709178fc513abc1b2670aa1ad2,7787,cajamar,SP,2018-05-10T10:56:27.000Z,397528cb28f94ec31114308697e6c43303279aa6099a747494aafe80333fb73b


In [0]:
%sql
SELECT
    customer_unique_id,
    customer_id,
    customer_zip_code_prefix,
    customer_city,
    customer_state,
    _event_timestamp,
    _change_id
FROM dev_customer360.silver.customer_current
WHERE customer_unique_id =
    '0000366f3b9a7992bf8c76cfdf3221e2';

customer_unique_id,customer_id,customer_zip_code_prefix,customer_city,customer_state,_event_timestamp,_change_id
0000366f3b9a7992bf8c76cfdf3221e2,fadbb3709178fc513abc1b2670aa1ad2,80010,curitiba,PR,2026-10-04T22:00:00.000Z,SIM_CUSTOMER_UPDATE_001


In [0]:
%sql
SELECT
    customer_unique_id,
    customer_zip_code_prefix,
    customer_city,
    customer_state,
    _event_timestamp,
    _change_id,
    __START_AT,
    __END_AT
FROM dev_customer360.silver.customer_history
WHERE customer_unique_id =
    '0000366f3b9a7992bf8c76cfdf3221e2'
ORDER BY __START_AT;

customer_unique_id,customer_zip_code_prefix,customer_city,customer_state,_event_timestamp,_change_id,__START_AT,__END_AT
0000366f3b9a7992bf8c76cfdf3221e2,7787,cajamar,SP,2018-05-10T10:56:27.000Z,397528cb28f94ec31114308697e6c43303279aa6099a747494aafe80333fb73b,1,2
0000366f3b9a7992bf8c76cfdf3221e2,80010,curitiba,PR,2026-10-04T22:00:00.000Z,SIM_CUSTOMER_UPDATE_001,2,null


In [0]:
import importlib
import config.schemas

importlib.reload(config.schemas)

from config.schemas import CUSTOMER_CDC_SIMULATOR_SCHEMA

from datetime import datetime
from pyspark.sql import Row

new_customer_id = "SIM_CUST_ID_001"
new_customer_unique_id = "SIM_CUST_UNIQUE_001"

customer_insert_df = spark.createDataFrame(
    [
        Row(
            customer_unique_id=new_customer_unique_id,
            customer_id=new_customer_id,
            customer_zip_code_prefix=110001,
            customer_city="new delhi",
            customer_state="DL",
            _operation="INSERT",
            _event_timestamp=datetime(2026, 10, 7, 19, 0, 0),
            _sequence_number=1,
            _change_id="SIM_CUSTOMER_INSERT_001"
        )
    ],
    schema=CUSTOMER_CDC_SIMULATOR_SCHEMA
)

display(customer_insert_df)

---------------------------------------------------------------------------
ModuleNotFoundError                       Traceback (most recent call last)
File <command-5279091500327022>, line 2
      1 import importlib
----> 2 import config.schemas
      4 importlib.reload(config.schemas)
      6 from config.schemas import CUSTOMER_CDC_SIMULATOR_SCHEMA

ModuleNotFoundError: No module named 'config'

In [0]:
from pyspark.sql.types import (
    StructType,
    StructField,
    StringType,
    IntegerType,
    LongType,
    TimestampType
)

CUSTOMER_CDC_SIMULATOR_SCHEMA = StructType([
    StructField("customer_unique_id", StringType(), False),
    StructField("customer_id", StringType(), True),
    StructField("customer_zip_code_prefix", IntegerType(), True),
    StructField("customer_city", StringType(), True),
    StructField("customer_state", StringType(), True),
    StructField("_operation", StringType(), False),
    StructField("_event_timestamp", TimestampType(), False),
    StructField("_sequence_number", LongType(), False),
    StructField("_change_id", StringType(), False),
])

print(CUSTOMER_CDC_SIMULATOR_SCHEMA.simpleString())

struct<customer_unique_id:string,customer_id:string,customer_zip_code_prefix:int,customer_city:string,customer_state:string,_operation:string,_event_timestamp:timestamp,_sequence_number:bigint,_change_id:string>


In [0]:
from datetime import datetime
from pyspark.sql import Row

customer_insert_df = spark.createDataFrame(
    [
        Row(
            customer_unique_id="SIM_CUST_UNIQUE_001",
            customer_id="SIM_CUST_ID_001",
            customer_zip_code_prefix=110001,
            customer_city="new delhi",
            customer_state="DL",
            _operation="INSERT",
            _event_timestamp=datetime(2026, 10, 7, 19, 0, 0),
            _sequence_number=1,
            _change_id="SIM_CUSTOMER_INSERT_001"
        )
    ],
    schema=CUSTOMER_CDC_SIMULATOR_SCHEMA
)

display(customer_insert_df)

customer_unique_id,customer_id,customer_zip_code_prefix,customer_city,customer_state,_operation,_event_timestamp,_sequence_number,_change_id
SIM_CUST_UNIQUE_001,SIM_CUST_ID_001,110001,new delhi,DL,INSERT,2026-10-07T19:00:00.000Z,1,SIM_CUSTOMER_INSERT_001


In [0]:
from pyspark.sql.functions import col, count, countDistinct

customer_insert_df.agg(
    count("*").alias("event_count"),
    countDistinct("_change_id").alias("unique_change_ids"),
    countDistinct("customer_unique_id").alias("customers")
).show()

invalid_events = (
    customer_insert_df
    .filter(
        col("customer_unique_id").isNull()
        | col("_operation").isNull()
        | (~col("_operation").isin("INSERT", "UPDATE", "DELETE"))
        | col("_event_timestamp").isNull()
        | col("_sequence_number").isNull()
        | col("_change_id").isNull()
    )
    .count()
)

print("Invalid simulator events:", invalid_events)

+-----------+-----------------+---------+
|event_count|unique_change_ids|customers|
+-----------+-----------------+---------+
|          1|                1|        1|
+-----------+-----------------+---------+

Invalid simulator events: 0


In [0]:
customer_simulator_path = (
    "/Volumes/dev_customer360/bronze/landing/"
    "cdc_simulator/customers"
)

(
    customer_insert_df
    .coalesce(1)
    .write
    .mode("append")
    .option("header", "true")
    .csv(customer_simulator_path)
)

print("Customer INSERT CDC event landed successfully.")

Customer INSERT CDC event landed successfully.


In [0]:
display(dbutils.fs.ls(customer_simulator_path))

path,name,size,modificationTime
dbfs:/Volumes/dev_customer360/bronze/landing/cdc_simulator/customers/_SUCCESS,_SUCCESS,0,1791380457000
dbfs:/Volumes/dev_customer360/bronze/landing/cdc_simulator/customers/_committed_8242434576744932485,_committed_8242434576744932485,113,1791380457000
dbfs:/Volumes/dev_customer360/bronze/landing/cdc_simulator/customers/_committed_968174682355327624,_committed_968174682355327624,112,1791131292000
dbfs:/Volumes/dev_customer360/bronze/landing/cdc_simulator/customers/_committed_vacuum2493204230457797926,_committed_vacuum2493204230457797926,95,1791380458000
dbfs:/Volumes/dev_customer360/bronze/landing/cdc_simulator/customers/_started_8242434576744932485,_started_8242434576744932485,0,1791380456000
dbfs:/Volumes/dev_customer360/bronze/landing/cdc_simulator/customers/part-00000-tid-8242434576744932485-89ba2c5b-70e7-4484-a071-5185bdfe8f75-132-1-c000.csv,part-00000-tid-8242434576744932485-89ba2c5b-70e7-4484-a071-5185bdfe8f75-132-1-c000.csv,255,1791380457000
dbfs:/Volumes/dev_customer360/bronze/landing/cdc_simulator/customers/part-00000-tid-968174682355327624-56953e5f-99b1-41ed-9b6c-c6d74ddb6eb6-177-1-c000.csv,part-00000-tid-968174682355327624-56953e5f-99b1-41ed-9b6c-c6d74ddb6eb6-177-1-c000.csv,283,1791131291000


In [0]:
%sql
SELECT
    customer_unique_id,
    customer_id,
    customer_zip_code_prefix,
    customer_city,
    customer_state,
    _operation,
    _event_timestamp,
    _sequence_number,
    _change_id
FROM dev_customer360.bronze.bronze_customer_cdc_simulated
ORDER BY _event_timestamp;

customer_unique_id,customer_id,customer_zip_code_prefix,customer_city,customer_state,_operation,_event_timestamp,_sequence_number,_change_id
0000366f3b9a7992bf8c76cfdf3221e2,fadbb3709178fc513abc1b2670aa1ad2,80010,curitiba,PR,UPDATE,2026-10-04T22:00:00.000Z,2,SIM_CUSTOMER_UPDATE_001
SIM_CUST_UNIQUE_001,SIM_CUST_ID_001,110001,new delhi,DL,INSERT,2026-10-07T19:00:00.000Z,1,SIM_CUSTOMER_INSERT_001


In [0]:
%sql
SELECT
    'SCD1_CURRENT' AS target,
    customer_unique_id,
    customer_id,
    customer_zip_code_prefix,
    customer_city,
    customer_state,
    _event_timestamp,
    _change_id,
    NULL AS __START_AT,
    NULL AS __END_AT
FROM dev_customer360.silver.customer_current
WHERE customer_unique_id = 'SIM_CUST_UNIQUE_001'

UNION ALL

SELECT
    'SCD2_HISTORY' AS target,
    customer_unique_id,
    customer_id,
    customer_zip_code_prefix,
    customer_city,
    customer_state,
    _event_timestamp,
    _change_id,
    __START_AT,
    __END_AT
FROM dev_customer360.silver.customer_history
WHERE customer_unique_id = 'SIM_CUST_UNIQUE_001';

target,customer_unique_id,customer_id,customer_zip_code_prefix,customer_city,customer_state,_event_timestamp,_change_id,__START_AT,__END_AT
SCD1_CURRENT,SIM_CUST_UNIQUE_001,SIM_CUST_ID_001,110001,new delhi,DL,2026-10-07T19:00:00.000Z,SIM_CUSTOMER_INSERT_001,null,null
SCD2_HISTORY,SIM_CUST_UNIQUE_001,SIM_CUST_ID_001,110001,new delhi,DL,2026-10-07T19:00:00.000Z,SIM_CUSTOMER_INSERT_001,1,null


In [0]:
from datetime import datetime
from pyspark.sql import Row

customer_delete_df = spark.createDataFrame(
    [
        Row(
            customer_unique_id="SIM_CUST_UNIQUE_001",
            customer_id="SIM_CUST_ID_001",

            # Profile values are not important for DELETE,
            # but we retain the latest known values for traceability.
            customer_zip_code_prefix=110001,
            customer_city="new delhi",
            customer_state="DL",

            _operation="DELETE",
            _event_timestamp=datetime(2026, 10, 7, 19, 15, 0),

            # INSERT was sequence 1, therefore DELETE = 2
            _sequence_number=2,

            _change_id="SIM_CUSTOMER_DELETE_001"
        )
    ],
    schema=CUSTOMER_CDC_SIMULATOR_SCHEMA
)

display(customer_delete_df)

customer_unique_id,customer_id,customer_zip_code_prefix,customer_city,customer_state,_operation,_event_timestamp,_sequence_number,_change_id
SIM_CUST_UNIQUE_001,SIM_CUST_ID_001,110001,new delhi,DL,DELETE,2026-10-07T19:15:00.000Z,2,SIM_CUSTOMER_DELETE_001


In [0]:
from pyspark.sql.functions import col, count, countDistinct

customer_delete_df.agg(
    count("*").alias("event_count"),
    countDistinct("_change_id").alias("unique_change_ids"),
    countDistinct("customer_unique_id").alias("customers")
).show()

invalid_events = (
    customer_delete_df
    .filter(
        col("customer_unique_id").isNull()
        | (col("_operation") != "DELETE")
        | col("_event_timestamp").isNull()
        | col("_sequence_number").isNull()
        | col("_change_id").isNull()
    )
    .count()
)

print("Invalid DELETE events:", invalid_events)

+-----------+-----------------+---------+
|event_count|unique_change_ids|customers|
+-----------+-----------------+---------+
|          1|                1|        1|
+-----------+-----------------+---------+

Invalid DELETE events: 0


In [0]:
customer_simulator_path = (
    "/Volumes/dev_customer360/bronze/landing/cdc_simulator/customers"
)

(
    customer_delete_df
    .coalesce(1)
    .write
    .mode("append")
    .option("header", "true")
    .csv(customer_simulator_path)
)

print("Customer DELETE CDC event landed successfully.")

Customer DELETE CDC event landed successfully.


In [0]:
files = [
    f for f in dbutils.fs.ls(customer_simulator_path) if f.name.endswith(".csv")
]
display(files)

path,name,size,modificationTime
dbfs:/Volumes/dev_customer360/bronze/landing/cdc_simulator/customers/part-00000-tid-4882517611517366317-d4b1b802-4557-493b-ba9d-de57147b2315-149-1-c000.csv,part-00000-tid-4882517611517366317-d4b1b802-4557-493b-ba9d-de57147b2315-149-1-c000.csv,255,1791381855000
dbfs:/Volumes/dev_customer360/bronze/landing/cdc_simulator/customers/part-00000-tid-8242434576744932485-89ba2c5b-70e7-4484-a071-5185bdfe8f75-132-1-c000.csv,part-00000-tid-8242434576744932485-89ba2c5b-70e7-4484-a071-5185bdfe8f75-132-1-c000.csv,255,1791380457000
dbfs:/Volumes/dev_customer360/bronze/landing/cdc_simulator/customers/part-00000-tid-968174682355327624-56953e5f-99b1-41ed-9b6c-c6d74ddb6eb6-177-1-c000.csv,part-00000-tid-968174682355327624-56953e5f-99b1-41ed-9b6c-c6d74ddb6eb6-177-1-c000.csv,283,1791131291000


In [0]:
%sql
SELECT
    customer_unique_id,
    _operation,
    _event_timestamp,
    _sequence_number,
    _change_id
FROM dev_customer360.bronze.bronze_customer_cdc_simulated
ORDER BY _event_timestamp;

customer_unique_id,_operation,_event_timestamp,_sequence_number,_change_id
0000366f3b9a7992bf8c76cfdf3221e2,UPDATE,2026-10-04T22:00:00.000Z,2,SIM_CUSTOMER_UPDATE_001
SIM_CUST_UNIQUE_001,INSERT,2026-10-07T19:00:00.000Z,1,SIM_CUSTOMER_INSERT_001
SIM_CUST_UNIQUE_001,DELETE,2026-10-07T19:15:00.000Z,2,SIM_CUSTOMER_DELETE_001


In [0]:
%sql
SELECT
    customer_unique_id,
    customer_id,
    customer_city,
    customer_state,
    _event_timestamp,
    _change_id
FROM dev_customer360.silver.customer_current
WHERE customer_unique_id = 'SIM_CUST_UNIQUE_001';

customer_unique_id,customer_id,customer_city,customer_state,_event_timestamp,_change_id


In [0]:
%sql
SELECT
    customer_unique_id,
    customer_id,
    customer_zip_code_prefix,
    customer_city,
    customer_state,
    _event_timestamp,
    _change_id,
    __START_AT,
    __END_AT
FROM dev_customer360.silver.customer_history
WHERE customer_unique_id = 'SIM_CUST_UNIQUE_001'
ORDER BY __START_AT;

customer_unique_id,customer_id,customer_zip_code_prefix,customer_city,customer_state,_event_timestamp,_change_id,__START_AT,__END_AT
SIM_CUST_UNIQUE_001,SIM_CUST_ID_001,110001,new delhi,DL,2026-10-07T19:00:00.000Z,SIM_CUSTOMER_INSERT_001,1,2


In [0]:
%sql
SELECT
    _change_id,
    COUNT(*) AS occurrence_count
FROM dev_customer360.bronze.bronze_customer_cdc_simulated
GROUP BY _change_id
HAVING COUNT(*) > 1;

_change_id,occurrence_count


In [0]:
%sql
SELECT
    COUNT(*) AS total_events,
    COUNT(DISTINCT _change_id) AS unique_change_ids
FROM dev_customer360.bronze.bronze_customer_cdc_simulated;

total_events,unique_change_ids
3,3


In [0]:
duplicate_insert_df = customer_insert_df

display(duplicate_insert_df)

customer_unique_id,customer_id,customer_zip_code_prefix,customer_city,customer_state,_operation,_event_timestamp,_sequence_number,_change_id
SIM_CUST_UNIQUE_001,SIM_CUST_ID_001,110001,new delhi,DL,INSERT,2026-10-07T19:00:00.000Z,1,SIM_CUSTOMER_INSERT_001


In [0]:
(
    duplicate_insert_df
    .coalesce(1)
    .write
    .mode("append")
    .option("header", "true")
    .csv(customer_simulator_path)
)

print("Duplicate CDC event landed as a new physical file.")

Duplicate CDC event landed as a new physical file.


In [0]:
files = [
    f for f in dbutils.fs.ls(customer_simulator_path)
    if f.name.endswith(".csv")
]

print("CSV file count:", len(files))
display(files)

CSV file count: 4


path,name,size,modificationTime
dbfs:/Volumes/dev_customer360/bronze/landing/cdc_simulator/customers/part-00000-tid-4882517611517366317-d4b1b802-4557-493b-ba9d-de57147b2315-149-1-c000.csv,part-00000-tid-4882517611517366317-d4b1b802-4557-493b-ba9d-de57147b2315-149-1-c000.csv,255,1791381855000
dbfs:/Volumes/dev_customer360/bronze/landing/cdc_simulator/customers/part-00000-tid-7216024953254499694-bfdc2c16-369a-4c20-b25c-047d2eaf3e60-191-1-c000.csv,part-00000-tid-7216024953254499694-bfdc2c16-369a-4c20-b25c-047d2eaf3e60-191-1-c000.csv,255,1791382549000
dbfs:/Volumes/dev_customer360/bronze/landing/cdc_simulator/customers/part-00000-tid-8242434576744932485-89ba2c5b-70e7-4484-a071-5185bdfe8f75-132-1-c000.csv,part-00000-tid-8242434576744932485-89ba2c5b-70e7-4484-a071-5185bdfe8f75-132-1-c000.csv,255,1791380457000
dbfs:/Volumes/dev_customer360/bronze/landing/cdc_simulator/customers/part-00000-tid-968174682355327624-56953e5f-99b1-41ed-9b6c-c6d74ddb6eb6-177-1-c000.csv,part-00000-tid-968174682355327624-56953e5f-99b1-41ed-9b6c-c6d74ddb6eb6-177-1-c000.csv,283,1791131291000


In [0]:
%sql
SELECT
    _change_id,
    COUNT(*) AS occurrence_count
FROM dev_customer360.bronze.bronze_customer_cdc_simulated
GROUP BY _change_id
ORDER BY occurrence_count DESC, _change_id;

_change_id,occurrence_count
SIM_CUSTOMER_INSERT_001,2
SIM_CUSTOMER_DELETE_001,1
SIM_CUSTOMER_UPDATE_001,1


In [0]:
%sql
SELECT
    COUNT(*) AS total_events,
    COUNT(DISTINCT _change_id) AS unique_change_ids
FROM dev_customer360.bronze.bronze_customer_cdc_simulated;

total_events,unique_change_ids
4,3


In [0]:
%sql
SELECT COUNT(*) AS current_rows
FROM dev_customer360.silver.customer_current
WHERE customer_unique_id = 'SIM_CUST_UNIQUE_001';

current_rows
0


In [0]:
%sql
SELECT
    customer_unique_id,
    customer_city,
    customer_state,
    _change_id,
    __START_AT,
    __END_AT
FROM dev_customer360.silver.customer_history
WHERE customer_unique_id = 'SIM_CUST_UNIQUE_001'
ORDER BY __START_AT;

customer_unique_id,customer_city,customer_state,_change_id,__START_AT,__END_AT
SIM_CUST_UNIQUE_001,new delhi,DL,SIM_CUSTOMER_INSERT_001,1,2


In [0]:
%sql
SELECT
    _change_id,
    _operation,
    _sequence_number,
    COUNT(*) AS occurrence_count
FROM dev_customer360.bronze.customer_cdc_deduplicated
GROUP BY
    _change_id,
    _operation,
    _sequence_number
ORDER BY _sequence_number, _change_id;

_change_id,_operation,_sequence_number,occurrence_count
SIM_CUSTOMER_INSERT_001,INSERT,1,1
SIM_CUSTOMER_DELETE_001,DELETE,2,1
SIM_CUSTOMER_UPDATE_001,UPDATE,2,1


In [0]:
%sql
SELECT
    COUNT(*) AS total_events,
    COUNT(DISTINCT _change_id) AS unique_change_ids,
    COUNT(*) - COUNT(DISTINCT _change_id) AS duplicate_events
FROM dev_customer360.bronze.customer_cdc_deduplicated;

total_events,unique_change_ids,duplicate_events
3,3,0


In [0]:
%sql
SELECT
    customer_unique_id,
    customer_zip_code_prefix,
    customer_city,
    customer_state,
    _event_timestamp,
    _change_id
FROM dev_customer360.silver.customer_current
WHERE customer_unique_id =
    '0000366f3b9a7992bf8c76cfdf3221e2';

customer_unique_id,customer_zip_code_prefix,customer_city,customer_state,_event_timestamp,_change_id
0000366f3b9a7992bf8c76cfdf3221e2,80010,curitiba,PR,2026-10-04T22:00:00.000Z,SIM_CUSTOMER_UPDATE_001


In [0]:
from pyspark.sql.types import (
    StructType,
    StructField,
    StringType,
    IntegerType,
    LongType,
    TimestampType
)

CUSTOMER_CDC_SIMULATOR_SCHEMA = StructType([
    StructField("customer_unique_id", StringType(), True),
    StructField("customer_id", StringType(), True),
    StructField("customer_zip_code_prefix", IntegerType(), True),
    StructField("customer_city", StringType(), True),
    StructField("customer_state", StringType(), True),
    StructField("_operation", StringType(), True),
    StructField("_event_timestamp", TimestampType(), True),
    StructField("_sequence_number", LongType(), True),
    StructField("_change_id", StringType(), True)
])

print(CUSTOMER_CDC_SIMULATOR_SCHEMA.simpleString())

struct<customer_unique_id:string,customer_id:string,customer_zip_code_prefix:int,customer_city:string,customer_state:string,_operation:string,_event_timestamp:timestamp,_sequence_number:bigint,_change_id:string>


In [0]:
from datetime import datetime
from pyspark.sql import Row

customer_out_of_order_df = spark.createDataFrame(
    [
        Row(
            customer_unique_id="0000366f3b9a7992bf8c76cfdf3221e2",
            customer_id="fadbb3709178fc513abc1b2670aa1ad2",
            customer_zip_code_prefix=400001,
            customer_city="mumbai",
            customer_state="MH",

            _operation="UPDATE",
            _event_timestamp=datetime(2026, 10, 3, 22, 0, 0),

            # Older than the already-processed sequence 2
            _sequence_number=1,

            # Unique event identity for this test
            _change_id="SIM_CUSTOMER_OUT_OF_ORDER_001"
        )
    ],
    schema=CUSTOMER_CDC_SIMULATOR_SCHEMA
)

display(customer_out_of_order_df)

customer_unique_id,customer_id,customer_zip_code_prefix,customer_city,customer_state,_operation,_event_timestamp,_sequence_number,_change_id
0000366f3b9a7992bf8c76cfdf3221e2,fadbb3709178fc513abc1b2670aa1ad2,400001,mumbai,MH,UPDATE,2026-10-03T22:00:00.000Z,1,SIM_CUSTOMER_OUT_OF_ORDER_001


In [0]:
customer_simulator_path = (
    "/Volumes/dev_customer360/bronze/landing/"
    "cdc_simulator/customers"
)

(
    customer_out_of_order_df
    .coalesce(1)
    .write
    .mode("append")
    .option("header", "true")
    .csv(customer_simulator_path)
)

print("Out-of-order customer CDC event landed successfully.")

Out-of-order customer CDC event landed successfully.


In [0]:
%sql
-- 1. Verify latest customer state (SCD Type 1)
SELECT
    customer_unique_id,
    customer_zip_code_prefix,
    customer_city,
    customer_state,
    _change_id
FROM dev_customer360.silver.customer_current
WHERE customer_unique_id =
    '0000366f3b9a7992bf8c76cfdf3221e2';

customer_unique_id,customer_zip_code_prefix,customer_city,customer_state,__START_AT,__END_AT
0000366f3b9a7992bf8c76cfdf3221e2,7787,cajamar,SP,1,2
0000366f3b9a7992bf8c76cfdf3221e2,80010,curitiba,PR,2,null


In [0]:
%sql
-- 2. Verify historical versions (SCD Type 2)
SELECT
    customer_unique_id,
    customer_zip_code_prefix,
    customer_city,
    customer_state,
    __START_AT,
    __END_AT
FROM dev_customer360.silver.customer_history
WHERE customer_unique_id =
    '0000366f3b9a7992bf8c76cfdf3221e2'
ORDER BY __START_AT;

customer_unique_id,customer_zip_code_prefix,customer_city,customer_state,__START_AT,__END_AT
0000366f3b9a7992bf8c76cfdf3221e2,7787,cajamar,SP,1,2
0000366f3b9a7992bf8c76cfdf3221e2,80010,curitiba,PR,2,null


In [0]:
%sql
SELECT
    customer_unique_id,
    customer_zip_code_prefix,
    customer_city,
    customer_state,
    _change_id
FROM dev_customer360.silver.customer_current
WHERE customer_unique_id =
    '0000366f3b9a7992bf8c76cfdf3221e2';

customer_unique_id,customer_zip_code_prefix,customer_city,customer_state,_change_id
0000366f3b9a7992bf8c76cfdf3221e2,80010,curitiba,PR,SIM_CUSTOMER_UPDATE_001


In [0]:
%sql
SELECT
    _change_id,
    _operation,
    _sequence_number,
    customer_city,
    customer_state,
    _event_timestamp,
    _ingestion_timestamp
FROM dev_customer360.bronze.bronze_customer_cdc_simulated
WHERE _change_id = 'SIM_CUSTOMER_OUT_OF_ORDER_001';

_change_id,_operation,_sequence_number,customer_city,customer_state,_event_timestamp,_ingestion_timestamp
SIM_CUSTOMER_OUT_OF_ORDER_001,UPDATE,1,mumbai,MH,2026-10-03T22:00:00.000Z,2026-10-10T08:39:22.110Z


In [0]:
%sql
SELECT
    customer_unique_id,
    COUNT(*) AS version_count,
    MIN(__START_AT) AS first_sequence,
    MAX(__START_AT) AS last_sequence
FROM dev_customer360.silver.customer_history
GROUP BY customer_unique_id
HAVING COUNT(*) >= 3
ORDER BY version_count DESC
LIMIT 10;

customer_unique_id,version_count,first_sequence,last_sequence
3e43e6105506432c953e165fb2acf44c,4,1,6
fe59d5878cd80080edbd29b5a0a4e1cf,3,1,3
9832ae2f7d3e5fa4c7a1a06e9551bc61,3,1,3
b9badb100ff8ecc16a403111209e3a06,3,1,3
47c1a3033b8b77b3ab6e109eb4d5fdf3,3,1,4
d44ccec15f5f86d14d6a2cfa67da1975,3,1,3


In [0]:
%sql
SELECT
    customer_unique_id,
    customer_id,
    customer_zip_code_prefix,
    customer_city,
    customer_state,
    __START_AT,
    __END_AT
FROM dev_customer360.silver.customer_history
WHERE customer_unique_id =
    '3e43e6105506432c953e165fb2acf44c'
ORDER BY __START_AT;

customer_unique_id,customer_id,customer_zip_code_prefix,customer_city,customer_state,__START_AT,__END_AT
3e43e6105506432c953e165fb2acf44c,06ec7aed3161859018db02f695b6600d,11701,praia grande,SP,1,2
3e43e6105506432c953e165fb2acf44c,a4413edae691fd0d28bd04b8a38b259d,11700,praia grande,SP,2,5
3e43e6105506432c953e165fb2acf44c,b63c9cfc5dcb06ed307ca95957fa216c,11704,praia grande,SP,5,6
3e43e6105506432c953e165fb2acf44c,2bbd32d4ef14893d2d8c1a0df08403cf,11701,praia grande,SP,6,null


In [0]:
%sql
SELECT
    customer_unique_id,
    customer_id,
    customer_zip_code_prefix,
    customer_city,
    customer_state,
    _operation,
    _sequence_number
FROM dev_customer360.bronze.bronze_customer_cdc
WHERE customer_unique_id =
    '3e43e6105506432c953e165fb2acf44c'
ORDER BY _sequence_number;

customer_unique_id,customer_id,customer_zip_code_prefix,customer_city,customer_state,_operation,_sequence_number
3e43e6105506432c953e165fb2acf44c,06ec7aed3161859018db02f695b6600d,11701,praia grande,SP,INSERT,1
3e43e6105506432c953e165fb2acf44c,a4413edae691fd0d28bd04b8a38b259d,11700,praia grande,SP,UPDATE,2
3e43e6105506432c953e165fb2acf44c,b63c9cfc5dcb06ed307ca95957fa216c,11704,praia grande,SP,UPDATE,5
3e43e6105506432c953e165fb2acf44c,2bbd32d4ef14893d2d8c1a0df08403cf,11701,praia grande,SP,UPDATE,6


In [0]:
%sql
SELECT
    _change_id,
    _operation,
    _sequence_number,
    customer_id,
    customer_city,
    customer_state
FROM dev_customer360.bronze.bronze_customer_cdc_simulated
WHERE customer_unique_id =
    '3e43e6105506432c953e165fb2acf44c'
ORDER BY _sequence_number;

_change_id,_operation,_sequence_number,customer_id,customer_city,customer_state


In [0]:
from pyspark.sql.types import (
    StructType,
    StructField,
    StringType,
    IntegerType,
    LongType,
    TimestampType
)

CUSTOMER_CDC_SIMULATOR_SCHEMA = StructType([
    StructField("customer_unique_id", StringType(), True),
    StructField("customer_id", StringType(), True),
    StructField("customer_zip_code_prefix", IntegerType(), True),
    StructField("customer_city", StringType(), True),
    StructField("customer_state", StringType(), True),
    StructField("_operation", StringType(), True),
    StructField("_event_timestamp", TimestampType(), True),
    StructField("_sequence_number", LongType(), True),
    StructField("_change_id", StringType(), True)
])

print(CUSTOMER_CDC_SIMULATOR_SCHEMA.simpleString())

struct<customer_unique_id:string,customer_id:string,customer_zip_code_prefix:int,customer_city:string,customer_state:string,_operation:string,_event_timestamp:timestamp,_sequence_number:bigint,_change_id:string>


In [0]:
from datetime import datetime
from pyspark.sql import Row

customer_late_arrival_df = spark.createDataFrame(
    [
        Row(
            customer_unique_id="3e43e6105506432c953e165fb2acf44c",
            customer_id="a4413edae691fd0d28bd04b8a38b259d",
            customer_zip_code_prefix=11703,
            customer_city="praia grande",
            customer_state="SP",
            _operation="UPDATE",
            _event_timestamp=datetime(2026, 10, 5, 12, 0, 0),
            _sequence_number=3,
            _change_id="SIM_CUSTOMER_LATE_ARRIVAL_001"
        )
    ],
    schema=CUSTOMER_CDC_SIMULATOR_SCHEMA
)

display(customer_late_arrival_df)


customer_unique_id,customer_id,customer_zip_code_prefix,customer_city,customer_state,_operation,_event_timestamp,_sequence_number,_change_id
3e43e6105506432c953e165fb2acf44c,a4413edae691fd0d28bd04b8a38b259d,11703,praia grande,SP,UPDATE,2026-10-05T12:00:00.000Z,3,SIM_CUSTOMER_LATE_ARRIVAL_001


In [0]:
customer_simulator_path = (
    "/Volumes/dev_customer360/bronze/landing/"
    "cdc_simulator/customers"
)

(
    customer_late_arrival_df
    .coalesce(1)
    .write
    .mode("append")
    .option("header", "true")
    .csv(customer_simulator_path)
)

print("Late-arriving customer CDC event landed successfully.")

Late-arriving customer CDC event landed successfully.


In [0]:
%sql
SELECT
    customer_unique_id,
    customer_id,
    customer_zip_code_prefix,
    customer_city,
    customer_state,
    _change_id
FROM dev_customer360.silver.customer_current
WHERE customer_unique_id =
    '3e43e6105506432c953e165fb2acf44c';

customer_unique_id,customer_id,customer_zip_code_prefix,customer_city,customer_state,_change_id
3e43e6105506432c953e165fb2acf44c,2bbd32d4ef14893d2d8c1a0df08403cf,11701,praia grande,SP,fbd23ba6b23064b3913a3463428f4ae69efe7edfeb025090273762d04ddc486c


In [0]:
%sql
SELECT
    customer_unique_id,
    customer_id,
    customer_zip_code_prefix,
    customer_city,
    customer_state,
    _change_id
FROM dev_customer360.silver.customer_current
WHERE customer_unique_id =
    '3e43e6105506432c953e165fb2acf44c';

customer_unique_id,customer_id,customer_zip_code_prefix,customer_city,customer_state,_change_id
3e43e6105506432c953e165fb2acf44c,2bbd32d4ef14893d2d8c1a0df08403cf,11701,praia grande,SP,fbd23ba6b23064b3913a3463428f4ae69efe7edfeb025090273762d04ddc486c


In [0]:
%sql
SELECT
    customer_unique_id,
    customer_zip_code_prefix,
    customer_city,
    __START_AT,
    __END_AT
FROM dev_customer360.silver.customer_history
WHERE customer_unique_id =
    '3e43e6105506432c953e165fb2acf44c'
ORDER BY __START_AT;

customer_unique_id,customer_zip_code_prefix,customer_city,__START_AT,__END_AT
3e43e6105506432c953e165fb2acf44c,11701,praia grande,1,2
3e43e6105506432c953e165fb2acf44c,11700,praia grande,2,3
3e43e6105506432c953e165fb2acf44c,11703,praia grande,3,5
3e43e6105506432c953e165fb2acf44c,11704,praia grande,5,6
3e43e6105506432c953e165fb2acf44c,11701,praia grande,6,null


In [0]:
%sql
WITH history_validation AS (
    SELECT
        customer_unique_id,
        __START_AT,
        __END_AT,

        LEAD(__START_AT) OVER (
            PARTITION BY customer_unique_id
            ORDER BY __START_AT
        ) AS next_start_at

    FROM dev_customer360.silver.customer_history
)

SELECT
    COUNT(*) AS total_versions,

    SUM(
        CASE
            WHEN __END_AT IS NOT NULL
             AND __END_AT <= __START_AT
            THEN 1 ELSE 0
        END
    ) AS invalid_intervals,

    SUM(
        CASE
            WHEN next_start_at IS NOT NULL
             AND (
                 __END_AT IS NULL
                 OR __END_AT > next_start_at
             )
            THEN 1 ELSE 0
        END
    ) AS overlapping_intervals,

    SUM(
        CASE
            WHEN next_start_at IS NULL
             AND __END_AT IS NULL
            THEN 1 ELSE 0
        END
    ) AS active_customer_versions

FROM history_validation;

total_versions,invalid_intervals,overlapping_intervals,active_customer_versions
96358,0,0,96096


In [0]:
%sql
WITH scd1 AS (
    SELECT
        COUNT(*) AS current_rows,
        COUNT(DISTINCT customer_unique_id) AS current_customers
    FROM dev_customer360.silver.customer_current
),
scd2 AS (
    SELECT
        COUNT(*) AS active_history_rows,
        COUNT(DISTINCT customer_unique_id) AS active_history_customers
    FROM dev_customer360.silver.customer_history
    WHERE __END_AT IS NULL
)
SELECT
    scd1.current_rows,
    scd1.current_customers,
    scd2.active_history_rows,
    scd2.active_history_customers,
    CASE
        WHEN scd1.current_rows = scd1.current_customers
         AND scd1.current_customers = scd2.active_history_customers
         AND scd2.active_history_rows = scd2.active_history_customers
        THEN 'PASS'
        ELSE 'FAIL'
    END AS reconciliation_status
FROM scd1
CROSS JOIN scd2;

current_rows,current_customers,active_history_rows,active_history_customers,reconciliation_status
96096,96096,96096,96096,PASS


In [0]:
%sql
DESCRIBE TABLE dev_customer360.bronze.bronze_order_cdc;

col_name,data_type,comment
order_id,string,null
customer_id,string,null
order_status,string,null
order_purchase_timestamp,timestamp,null
order_approved_at,timestamp,null
order_delivered_carrier_date,timestamp,null
order_delivered_customer_date,timestamp,null
order_estimated_delivery_date,timestamp,null
_event_type,string,null
_lifecycle_rank,int,null


In [0]:
%sql
SELECT
    _event_type,
    _operation,
    _lifecycle_rank,
    MIN(_sequence_number) AS min_sequence,
    MAX(_sequence_number) AS max_sequence,
    COUNT(*) AS total_events
FROM dev_customer360.bronze.bronze_order_cdc
GROUP BY
    _event_type,
    _operation,
    _lifecycle_rank
ORDER BY
    _lifecycle_rank,
    _event_type;

_event_type,_operation,_lifecycle_rank,min_sequence,max_sequence,total_events
PURCHASED,INSERT,1,1,1,99441
APPROVED,UPDATE,2,2,4,99281
SHIPPED,UPDATE,3,2,4,97492
DELIVERED,UPDATE,4,3,4,96476


In [0]:
%sql
WITH complete_orders AS (
    SELECT
        order_id
    FROM dev_customer360.bronze.bronze_order_cdc
    GROUP BY order_id
    HAVING COUNT(DISTINCT _event_type) = 4
)

SELECT
    c.order_id,
    c.customer_id,
    c.order_status,
    c._event_type,
    c._lifecycle_rank,
    c._sequence_number,
    c._operation,
    c._event_timestamp
FROM dev_customer360.bronze.bronze_order_cdc c
INNER JOIN (
    SELECT order_id
    FROM complete_orders
    ORDER BY order_id
    LIMIT 1
) o
    ON c.order_id = o.order_id
ORDER BY c._sequence_number;

order_id,customer_id,order_status,_event_type,_lifecycle_rank,_sequence_number,_operation,_event_timestamp
00010242fe8c5a6d1ba2dd792cb16214,3ce436f183e68e07877b285a838db11a,purchased,PURCHASED,1,1,INSERT,2017-09-13T08:59:02.000Z
00010242fe8c5a6d1ba2dd792cb16214,3ce436f183e68e07877b285a838db11a,approved,APPROVED,2,2,UPDATE,2017-09-13T09:45:35.000Z
00010242fe8c5a6d1ba2dd792cb16214,3ce436f183e68e07877b285a838db11a,shipped,SHIPPED,3,3,UPDATE,2017-09-19T18:34:16.000Z
00010242fe8c5a6d1ba2dd792cb16214,3ce436f183e68e07877b285a838db11a,delivered,DELIVERED,4,4,UPDATE,2017-09-20T23:43:48.000Z


In [0]:
%sql
WITH latest_bronze_event AS (
    SELECT
        order_id,
        _sequence_number,
        _event_type,
        ROW_NUMBER() OVER (
            PARTITION BY order_id
            ORDER BY _sequence_number DESC
        ) AS rn
    FROM dev_customer360.bronze.bronze_order_cdc
)

SELECT
    s.order_id,
    s.customer_id,
    s.order_status,
    s.order_purchase_timestamp,
    s.order_approved_at,
    s.order_delivered_carrier_date,
    s.order_delivered_customer_date,
    b._sequence_number AS latest_sequence,
    b._event_type AS latest_lifecycle_event,
    s._change_id
FROM dev_customer360.silver.order_current s
INNER JOIN latest_bronze_event b
    ON s.order_id = b.order_id
   AND b.rn = 1
WHERE LOWER(s.order_status) IN (
    'created',
    'approved',
    'processing'
)
ORDER BY s.order_purchase_timestamp DESC
LIMIT 10;

order_id,customer_id,order_status,order_purchase_timestamp,order_approved_at,order_delivered_carrier_date,order_delivered_customer_date,latest_sequence,latest_lifecycle_event,_change_id
ded456690bcb2ffd4def86541479037f,e72188520e7450d41369c84fed0a4b68,approved,2018-08-24T06:58:50.000Z,2018-08-24T11:45:18.000Z,null,null,2,APPROVED,173fc36a18a7c080c80878bb871da9582d9cb670215b1ba3418d021a45d5e804
02de1e44936e56ddc1621c46d86bf91e,c4c369211d1aaab90c8e097f6939dda2,approved,2018-08-21T12:21:00.000Z,2018-08-21T12:35:12.000Z,null,null,2,APPROVED,268db100fa563aeb54fbbcf513b1914757a6d3b3981c04ebc61d5fce1dc8913b
acfa87544c19d596707d25cf2f7dab61,d5feeb223000c4c6dfdb7219b681e1d4,approved,2018-08-17T00:55:54.000Z,2018-08-18T00:50:11.000Z,null,null,2,APPROVED,866267886b5e12167ce55ba14bc5e6d132c8a6e211a6de9fa8d41a64f60c8756
54ee4ac3ad09faa2237f8a844b4d7b92,502de0f9e9835ab231c2851acd163376,approved,2018-08-16T19:28:02.000Z,2018-08-16T19:49:29.000Z,null,null,2,APPROVED,3417998b37229df1a9b1fde0eb8add83dba911f10a311586df932b3f7a120391
a9491b6c990bc3b79967c5f058e46d8f,ef1615358c72dae1c068aedc495a13f3,approved,2018-08-16T13:07:32.000Z,2018-08-16T13:23:58.000Z,null,null,2,APPROVED,50a5b5a7b51dac5298b1ce56dd624b3aa0ec3d88a2668401ce67e050cbdc8117
77afc8cdc7d93975016850b0b1b02c90,6478510b2c0573351a3bf335b4635c34,approved,2018-08-15T22:39:11.000Z,2018-08-15T22:50:16.000Z,null,null,2,APPROVED,29c5fcf52d94d4d67b2a7367344ccc7e6c465c059550aa57cb63e0b65da0890d
00310b0c75bb13015ec4d82d341865a4,0dad07848c618cc5a4679a1bfe1db8d2,approved,2018-08-15T14:29:08.000Z,2018-08-15T15:04:25.000Z,null,null,2,APPROVED,9f6770210271c702232ac37e3b86f8a87ba1d0cc41cfab8eb27205d6a1ebff7b
c3fd18a4aeb8e2d589b0248ce60e91b7,17c867817e32d1474241a11bb120d4c4,approved,2018-08-14T18:45:08.000Z,2018-08-14T19:05:23.000Z,null,null,2,APPROVED,211a3ce10e7d92b374c9920161efec43d960a9769a3e66978b05323995d9f542
749309f96df588c96621963117e9530f,7cbca7bfacc12d22b0c5ec54733013d0,approved,2018-08-14T17:57:15.000Z,2018-08-14T18:25:19.000Z,null,null,2,APPROVED,7556b085b4db44aafeb60c83306273ac5d3ecbad3717763364d8e00fd1d656dd
83630f2412ec5ad7dc40991d1225e93c,ad6d2a29482345c8f02cc58311e11312,approved,2018-08-14T15:26:11.000Z,2018-08-14T15:44:11.000Z,null,null,2,APPROVED,7213ef0cf15d04ac341dc7fd55d8f2c89ab42ded50b62182fac66d451124c584


In [0]:
%sql
SELECT
    order_id,
    customer_id,
    order_status,
    order_purchase_timestamp,
    order_approved_at,
    order_delivered_carrier_date,
    order_delivered_customer_date,
    order_estimated_delivery_date
FROM dev_customer360.silver.order_current
WHERE order_id = 'ded456690bcb2ffd4def86541479037f';

order_id,customer_id,order_status,order_purchase_timestamp,order_approved_at,order_delivered_carrier_date,order_delivered_customer_date,order_estimated_delivery_date
ded456690bcb2ffd4def86541479037f,e72188520e7450d41369c84fed0a4b68,approved,2018-08-24T06:58:50.000Z,2018-08-24T11:45:18.000Z,null,null,2018-08-29T00:00:00.000Z


In [0]:
from pyspark.sql.types import (
    StructType,
    StructField,
    StringType,
    IntegerType,
    LongType,
    TimestampType
)

ORDER_CDC_SIMULATOR_SCHEMA = StructType([
    StructField("order_id", StringType(), True),
    StructField("customer_id", StringType(), True),
    StructField("order_status", StringType(), True),

    StructField("order_purchase_timestamp", TimestampType(), True),
    StructField("order_approved_at", TimestampType(), True),
    StructField("order_delivered_carrier_date", TimestampType(), True),
    StructField("order_delivered_customer_date", TimestampType(), True),
    StructField("order_estimated_delivery_date", TimestampType(), True),

    StructField("_event_type", StringType(), True),
    StructField("_lifecycle_rank", IntegerType(), True),
    StructField("_event_timestamp", TimestampType(), True),

    StructField("_sequence_number", LongType(), True),
    StructField("_operation", StringType(), True),
    StructField("_change_id", StringType(), True)
])

In [0]:
print(ORDER_CDC_SIMULATOR_SCHEMA.simpleString())

struct<order_id:string,customer_id:string,order_status:string,order_purchase_timestamp:timestamp,order_approved_at:timestamp,order_delivered_carrier_date:timestamp,order_delivered_customer_date:timestamp,order_estimated_delivery_date:timestamp,_event_type:string,_lifecycle_rank:int,_event_timestamp:timestamp,_sequence_number:bigint,_operation:string,_change_id:string>


In [0]:
from pathlib import Path

schema_file = Path(
    "/Workspace/Users/karayatprabhakar@gmail.com/"
    "customer360/config/schemas.py"
)

content = schema_file.read_text()

print("File exists:", schema_file.exists())
print(
    "ORDER_CDC_SIMULATOR_SCHEMA defined:",
    "ORDER_CDC_SIMULATOR_SCHEMA" in content
)

print("\nLast 1500 characters of schemas.py:")
print(content[-1500:])

File exists: True
ORDER_CDC_SIMULATOR_SCHEMA defined: False

Last 1500 characters of schemas.py:
e_prefix", IntegerType(), True),
    StructField("geolocation_lat", DoubleType(), True),
    StructField("geolocation_lng", DoubleType(), True),
    StructField("geolocation_city", StringType(), True),
    StructField("geolocation_state", StringType(), True)
])


# ============================================================
# CATEGORY TRANSLATION
# ============================================================

CATEGORY_TRANSLATION_SCHEMA = StructType([
    StructField("product_category_name", StringType(), True),
    StructField("product_category_name_english", StringType(), True)
])


SCHEMA_REGISTRY = {
    "customers": CUSTOMERS_SCHEMA,
    "orders": ORDERS_SCHEMA,
    "order_items": ORDER_ITEMS_SCHEMA,
    "payments": PAYMENTS_SCHEMA,
    "reviews": REVIEWS_SCHEMA,
    "products": PRODUCTS_SCHEMA,
    "sellers": SELLERS_SCHEMA,
    "geolocation": GEOLOCATION_SCHEMA,
    "category_transl

In [0]:
import importlib
import config.schemas as schemas

# Reload the latest saved version
importlib.invalidate_caches()
importlib.reload(schemas)

# Check whether the schema is available
print("Module path:", schemas.__file__)
print(
    "Schema exists:",
    hasattr(schemas, "ORDER_CDC_SIMULATOR_SCHEMA")
)

---------------------------------------------------------------------------
ModuleNotFoundError                       Traceback (most recent call last)
File <command-8583013144810006>, line 2
      1 import importlib
----> 2 import config.schemas as schemas
      4 # Reload the latest saved version
      5 importlib.invalidate_caches()

ModuleNotFoundError: No module named 'config'

In [0]:
import importlib
import config.schemas as schemas

importlib.invalidate_caches()
importlib.reload(schemas)

print(
    "Order CDC schema available:",
    hasattr(schemas, "ORDER_CDC_SIMULATOR_SCHEMA")
)

print(
    "Total columns:",
    len(schemas.ORDER_CDC_SIMULATOR_SCHEMA.fields)
)

print(
    "Sequence data type:",
    schemas.ORDER_CDC_SIMULATOR_SCHEMA[
        "_sequence_number"
    ].dataType.simpleString()
)

---------------------------------------------------------------------------
ModuleNotFoundError                       Traceback (most recent call last)
File <command-8583013144810007>, line 2
      1 import importlib
----> 2 import config.schemas as schemas
      4 importlib.invalidate_caches()
      5 importlib.reload(schemas)

ModuleNotFoundError: No module named 'config'

In [0]:
import importlib
import config.ingestion_config as ingestion_config

importlib.invalidate_caches()
importlib.reload(ingestion_config)

config = ingestion_config.ORDER_CDC_SIMULATOR_CONFIG

print("Entity:", config.entity_name)
print("Source system:", config.source_system)
print("Source path:", config.source_path)
print("Target table:", config.target_table)
print("File format:", config.file_format)
print("Schema columns:", len(config.schema.fields))
print("Business columns:", len(config.business_columns))

---------------------------------------------------------------------------
ModuleNotFoundError                       Traceback (most recent call last)
File <command-8583013144810009>, line 2
      1 import importlib
----> 2 import config.ingestion_config as ingestion_config
      4 importlib.invalidate_caches()
      5 importlib.reload(ingestion_config)

ModuleNotFoundError: No module named 'config'

In [0]:
%sql
DESCRIBE TABLE dev_customer360.bronze.bronze_order_cdc_simulated;

col_name,data_type,comment
order_id,string,null
customer_id,string,null
order_status,string,null
order_purchase_timestamp,timestamp,null
order_approved_at,timestamp,null
order_delivered_carrier_date,timestamp,null
order_delivered_customer_date,timestamp,null
order_estimated_delivery_date,timestamp,null
_event_type,string,null
_lifecycle_rank,int,null


In [0]:
%sql
SELECT COUNT(*) AS total_rows
FROM dev_customer360.bronze.bronze_order_cdc_simulated;

total_rows
0


In [0]:
%sql
SELECT
    order_id,
    customer_id,
    order_status,
    order_purchase_timestamp,
    order_approved_at,
    order_delivered_carrier_date,
    order_delivered_customer_date,
    order_estimated_delivery_date
FROM dev_customer360.silver.order_current
WHERE order_id = 'ded456690bcb2ffd4def86541479037f';

order_id,customer_id,order_status,order_purchase_timestamp,order_approved_at,order_delivered_carrier_date,order_delivered_customer_date,order_estimated_delivery_date
ded456690bcb2ffd4def86541479037f,e72188520e7450d41369c84fed0a4b68,approved,2018-08-24T06:58:50.000Z,2018-08-24T11:45:18.000Z,null,null,2018-08-29T00:00:00.000Z


In [0]:
from datetime import datetime
from uuid import uuid4

from pyspark.sql import Row

order_id = "ded456690bcb2ffd4def86541479037f"

source = (
    spark.table("dev_customer360.silver.order_current")
    .filter(f"order_id = '{order_id}'")
    .select(
        "order_id",
        "customer_id",
        "order_status",
        "order_purchase_timestamp",
        "order_approved_at",
        "order_delivered_carrier_date",
        "order_delivered_customer_date",
        "order_estimated_delivery_date"
    )
    .collect()
)

assert len(source) == 1, "Expected exactly one current order"

order = source[0]

assert order.order_status == "approved"
assert order.order_delivered_carrier_date is None
assert order.order_delivered_customer_date is None

shipping_time = datetime(2018, 8, 25, 10, 30, 0)

event = Row(
    order_id=order.order_id,
    customer_id=order.customer_id,
    order_status="shipped",
    order_purchase_timestamp=order.order_purchase_timestamp,
    order_approved_at=order.order_approved_at,
    order_delivered_carrier_date=shipping_time,
    order_delivered_customer_date=None,
    order_estimated_delivery_date=order.order_estimated_delivery_date,
    _event_type="SHIPPED",
    _lifecycle_rank=3,
    _event_timestamp=shipping_time,
    _sequence_number=3,
    _operation="UPDATE",
    _change_id=f"SIM_ORDER_SHIPPED_{uuid4().hex}"
)

event_df = spark.createDataFrame(
    [event],
    schema=ORDER_CDC_SIMULATOR_SCHEMA
)

display(event_df)

order_id,customer_id,order_status,order_purchase_timestamp,order_approved_at,order_delivered_carrier_date,order_delivered_customer_date,order_estimated_delivery_date,_event_type,_lifecycle_rank,_event_timestamp,_sequence_number,_operation,_change_id
ded456690bcb2ffd4def86541479037f,e72188520e7450d41369c84fed0a4b68,shipped,2018-08-24T06:58:50.000Z,2018-08-24T11:45:18.000Z,2018-08-25T10:30:00.000Z,null,2018-08-29T00:00:00.000Z,SHIPPED,3,2018-08-25T10:30:00.000Z,3,UPDATE,SIM_ORDER_SHIPPED_db79d0184e05405387a8003bb8994112


In [0]:
from uuid import uuid4

landing_path = (
    "/Volumes/dev_customer360/bronze/landing/"
    "cdc_simulator/orders"
)

batch_id = uuid4().hex

output_path = f"{landing_path}/batch_{batch_id}"

(
    event_df
    .coalesce(1)
    .write
    .mode("append")
    .option("header", "true")
    .option("timestampFormat", "yyyy-MM-dd'T'HH:mm:ss.SSSXXX")
    .csv(output_path)
)

print("CDC event written successfully")
print("Output path:", output_path)
print("Change ID:", event_df.select("_change_id").first()[0])

CDC event written successfully
Output path: /Volumes/dev_customer360/bronze/landing/cdc_simulator/orders/batch_91fceac1fedd4cf787d7f598e3575aa2
Change ID: SIM_ORDER_SHIPPED_db79d0184e05405387a8003bb8994112


In [0]:
%sql
SELECT
    order_id,
    order_status,
    _event_type,
    _lifecycle_rank,
    _sequence_number,
    _operation,
    _change_id,
    _source_file_name,
    _rescued_data
FROM dev_customer360.bronze.bronze_order_cdc_simulated
WHERE _change_id =
    'SIM_ORDER_SHIPPED_db79d0184e05405387a8003bb8994112';

order_id,order_status,_event_type,_lifecycle_rank,_sequence_number,_operation,_change_id,_source_file_name,_rescued_data
ded456690bcb2ffd4def86541479037f,shipped,SHIPPED,3,3,UPDATE,SIM_ORDER_SHIPPED_db79d0184e05405387a8003bb8994112,part-00000-tid-7482670809728876596-6674dd19-485b-4dde-ac16-4a6a5ea3eb6c-211-1-c000.csv,null


In [0]:
%sql
SELECT
    _change_id,
    COUNT(*) AS event_count
FROM dev_customer360.bronze.bronze_order_cdc_simulated
WHERE _change_id =
    'SIM_ORDER_SHIPPED_db79d0184e05405387a8003bb8994112'
GROUP BY _change_id;

_change_id,event_count
SIM_ORDER_SHIPPED_db79d0184e05405387a8003bb8994112,1


In [0]:
%sql
SELECT
    order_id,
    order_status,
    order_delivered_carrier_date,
    _event_type,
    _change_id
FROM dev_customer360.silver.order_current
WHERE order_id = 'ded456690bcb2ffd4def86541479037f';

order_id,order_status,order_delivered_carrier_date,_event_type,_change_id
ded456690bcb2ffd4def86541479037f,shipped,2018-08-25T10:30:00.000Z,SHIPPED,SIM_ORDER_SHIPPED_db79d0184e05405387a8003bb8994112


In [0]:
%sql
SELECT
    order_id,
    order_status,
    _event_type,
    __START_AT,
    __END_AT
FROM dev_customer360.silver.order_history
WHERE order_id = 'ded456690bcb2ffd4def86541479037f'
ORDER BY __START_AT;

order_id,order_status,_event_type,__START_AT,__END_AT
ded456690bcb2ffd4def86541479037f,purchased,PURCHASED,1,2
ded456690bcb2ffd4def86541479037f,approved,APPROVED,2,3
ded456690bcb2ffd4def86541479037f,shipped,SHIPPED,3,null


In [0]:
%sql
SELECT
    order_id,
    COUNT(*) AS total_versions,
    SUM(
        CASE WHEN __END_AT IS NULL THEN 1 ELSE 0 END
    ) AS active_versions,
    COUNT(DISTINCT __START_AT) AS distinct_sequences
FROM dev_customer360.silver.order_history
WHERE order_id = 'ded456690bcb2ffd4def86541479037f'
GROUP BY order_id;

order_id,total_versions,active_versions,distinct_sequences
ded456690bcb2ffd4def86541479037f,3,1,3


In [0]:
%sql
SELECT
    _change_id,
    COUNT(*) AS bronze_event_count
FROM dev_customer360.bronze.bronze_order_cdc_simulated
WHERE _change_id =
    'SIM_ORDER_SHIPPED_db79d0184e05405387a8003bb8994112'
GROUP BY _change_id;

_change_id,bronze_event_count
SIM_ORDER_SHIPPED_db79d0184e05405387a8003bb8994112,1


In [0]:
change_id = (
    "SIM_ORDER_SHIPPED_"
    "db79d0184e05405387a8003bb8994112"
)

source_df = (
    spark.table(
        "dev_customer360.bronze.bronze_order_cdc_simulated"
    )
    .filter(f"_change_id = '{change_id}'")
)

assert source_df.count() == 1, (
    "Expected exactly one original CDC event"
)

# Select the original 14 CDC columns.
# Exclude Auto Loader and ingestion metadata.
cdc_columns = [
    "order_id",
    "customer_id",
    "order_status",
    "order_purchase_timestamp",
    "order_approved_at",
    "order_delivered_carrier_date",
    "order_delivered_customer_date",
    "order_estimated_delivery_date",
    "_event_type",
    "_lifecycle_rank",
    "_event_timestamp",
    "_sequence_number",
    "_operation",
    "_change_id",
]

duplicate_df = source_df.select(*cdc_columns)

assert duplicate_df.count() == 1

display(duplicate_df)

order_id,customer_id,order_status,order_purchase_timestamp,order_approved_at,order_delivered_carrier_date,order_delivered_customer_date,order_estimated_delivery_date,_event_type,_lifecycle_rank,_event_timestamp,_sequence_number,_operation,_change_id
ded456690bcb2ffd4def86541479037f,e72188520e7450d41369c84fed0a4b68,shipped,2018-08-24T06:58:50.000Z,2018-08-24T11:45:18.000Z,2018-08-25T10:30:00.000Z,null,2018-08-29T00:00:00.000Z,SHIPPED,3,2018-08-25T10:30:00.000Z,3,UPDATE,SIM_ORDER_SHIPPED_db79d0184e05405387a8003bb8994112


In [0]:
from uuid import uuid4

landing_path = (
    "/Volumes/dev_customer360/bronze/landing/"
    "cdc_simulator/orders"
)

batch_id = uuid4().hex
duplicate_path = f"{landing_path}/duplicate_batch_{batch_id}"

(
    duplicate_df
    .coalesce(1)
    .write
    .mode("append")
    .option("header", "true")
    .option("timestampFormat", "yyyy-MM-dd'T'HH:mm:ss.SSSXXX")
    .csv(duplicate_path)
)

print("Duplicate CDC event written successfully")
print("Output path:", duplicate_path)
print("Change ID:", duplicate_df.select("_change_id").first()[0])

Duplicate CDC event written successfully
Output path: /Volumes/dev_customer360/bronze/landing/cdc_simulator/orders/duplicate_batch_34cda0538d8e42b0b3e98a40da032d24
Change ID: SIM_ORDER_SHIPPED_db79d0184e05405387a8003bb8994112


In [0]:
%sql
SELECT
    _change_id,
    COUNT(*) AS bronze_event_count,
    COUNT(DISTINCT _source_file_path) AS distinct_source_files
FROM dev_customer360.bronze.bronze_order_cdc_simulated
WHERE _change_id =
    'SIM_ORDER_SHIPPED_db79d0184e05405387a8003bb8994112'
GROUP BY _change_id;

_change_id,bronze_event_count,distinct_source_files
SIM_ORDER_SHIPPED_db79d0184e05405387a8003bb8994112,2,2


In [0]:
%sql
SELECT
    order_id,
    order_status,
    _event_type,
    _change_id
FROM dev_customer360.silver.order_current
WHERE order_id = 'ded456690bcb2ffd4def86541479037f';

order_id,order_status,_event_type,_change_id
ded456690bcb2ffd4def86541479037f,shipped,SHIPPED,SIM_ORDER_SHIPPED_db79d0184e05405387a8003bb8994112


In [0]:
%sql
SELECT
    order_status,
    _event_type,
    __START_AT,
    __END_AT
FROM dev_customer360.silver.order_history
WHERE order_id = 'ded456690bcb2ffd4def86541479037f'
ORDER BY __START_AT;

order_status,_event_type,__START_AT,__END_AT
purchased,PURCHASED,1,2
approved,APPROVED,2,3
shipped,SHIPPED,3,null


In [0]:
%sql
SELECT
    order_id,
    _event_type,
    _sequence_number,
    _operation,
    _change_id
FROM dev_customer360.bronze.bronze_order_cdc
WHERE order_id = 'ded456690bcb2ffd4def86541479037f'
ORDER BY _sequence_number;

order_id,_event_type,_sequence_number,_operation,_change_id
ded456690bcb2ffd4def86541479037f,PURCHASED,1,INSERT,311ac3e664fb773059fc0a0479844bf107f9997827054920c77e480366c4b3b2
ded456690bcb2ffd4def86541479037f,APPROVED,2,UPDATE,173fc36a18a7c080c80878bb871da9582d9cb670215b1ba3418d021a45d5e804


In [0]:
from pyspark.sql import functions as F

order_id = "ded456690bcb2ffd4def86541479037f"

historical_df = (
    spark.table("dev_customer360.bronze.bronze_order_cdc")
    .filter(
        (F.col("order_id") == order_id) &
        (F.col("_sequence_number") == 2)
    )
)

assert historical_df.count() == 1

cdc_columns = [
    "order_id",
    "customer_id",
    "order_status",
    "order_purchase_timestamp",
    "order_approved_at",
    "order_delivered_carrier_date",
    "order_delivered_customer_date",
    "order_estimated_delivery_date",
    "_event_type",
    "_lifecycle_rank",
    "_event_timestamp",
    "_sequence_number",
    "_operation",
    "_change_id",
]

stale_event_df = historical_df.select(*cdc_columns)

display(stale_event_df)

order_id,customer_id,order_status,order_purchase_timestamp,order_approved_at,order_delivered_carrier_date,order_delivered_customer_date,order_estimated_delivery_date,_event_type,_lifecycle_rank,_event_timestamp,_sequence_number,_operation,_change_id
ded456690bcb2ffd4def86541479037f,e72188520e7450d41369c84fed0a4b68,approved,2018-08-24T06:58:50.000Z,2018-08-24T11:45:18.000Z,null,null,2018-08-29T00:00:00.000Z,APPROVED,2,2018-08-24T11:45:18.000Z,2,UPDATE,173fc36a18a7c080c80878bb871da9582d9cb670215b1ba3418d021a45d5e804


In [0]:
from uuid import uuid4

landing_path = (
    "/Volumes/dev_customer360/bronze/landing/"
    "cdc_simulator/orders"
)

batch_id = uuid4().hex

stale_event_path = (
    f"{landing_path}/stale_approved_batch_{batch_id}"
)

(
    stale_event_df
    .coalesce(1)
    .write
    .mode("append")
    .option("header", "true")
    .option(
        "timestampFormat",
        "yyyy-MM-dd'T'HH:mm:ss.SSSXXX"
    )
    .csv(stale_event_path)
)

print("Stale APPROVED event written successfully")
print("Output path:", stale_event_path)
print(
    "Change ID:",
    stale_event_df.select("_change_id").first()[0]
)

Stale APPROVED event written successfully
Output path: /Volumes/dev_customer360/bronze/landing/cdc_simulator/orders/stale_approved_batch_518a3e726aa94555bb3d6052f8fea8c0
Change ID: 173fc36a18a7c080c80878bb871da9582d9cb670215b1ba3418d021a45d5e804


In [0]:
%sql
SELECT
    _change_id,
    _event_type,
    _sequence_number,
    COUNT(*) AS bronze_event_count
FROM dev_customer360.bronze.bronze_order_cdc_simulated
WHERE _change_id =
    '173fc36a18a7c080c80878bb871da9582d9cb670215b1ba3418d021a45d5e804'
GROUP BY
    _change_id,
    _event_type,
    _sequence_number;

_change_id,_event_type,_sequence_number,bronze_event_count
173fc36a18a7c080c80878bb871da9582d9cb670215b1ba3418d021a45d5e804,APPROVED,2,1


In [0]:
%sql
SELECT
    order_id,
    order_status,
    _event_type,
    _change_id
FROM dev_customer360.silver.order_current
WHERE order_id = 'ded456690bcb2ffd4def86541479037f';

order_id,order_status,_event_type,_change_id
ded456690bcb2ffd4def86541479037f,shipped,SHIPPED,SIM_ORDER_SHIPPED_db79d0184e05405387a8003bb8994112


In [0]:
%sql
SELECT
    order_status,
    _event_type,
    __START_AT,
    __END_AT
FROM dev_customer360.silver.order_history
WHERE order_id = 'ded456690bcb2ffd4def86541479037f'
ORDER BY __START_AT;

order_status,_event_type,__START_AT,__END_AT
purchased,PURCHASED,1,2
approved,APPROVED,2,3
shipped,SHIPPED,3,null


In [0]:
%sql
SELECT
    order_id,
    COUNT(*) AS historical_events,
    MIN(_sequence_number) AS min_sequence,
    MAX(_sequence_number) AS max_sequence,
    COLLECT_LIST(
        CONCAT(
            _event_type,
            ':',
            CAST(_sequence_number AS STRING)
        )
    ) AS lifecycle_events
FROM dev_customer360.bronze.bronze_order_cdc
GROUP BY order_id
HAVING COUNT(*) >= 2
ORDER BY historical_events ASC, order_id
LIMIT 10;

order_id,historical_events,min_sequence,max_sequence,lifecycle_events
0010dedd556712d7bb69a19cb7bbd37a,2,1,2,"List(PURCHASED:1, APPROVED:2)"
00310b0c75bb13015ec4d82d341865a4,2,1,2,"List(PURCHASED:1, APPROVED:2)"
00a500bc03bc4ec968e574c2553bed4b,2,1,2,"List(PURCHASED:1, APPROVED:2)"
00ae7a8b4936674ebb701d4a23719a79,2,1,2,"List(PURCHASED:1, APPROVED:2)"
00bca4adac549020c1273714d04d0208,2,1,2,"List(PURCHASED:1, APPROVED:2)"
00daac8efd71674d62356c2a306d1e4c,2,1,2,"List(PURCHASED:1, APPROVED:2)"
00ff0cf5583758e6964723e42f111bf4,2,1,2,"List(PURCHASED:1, APPROVED:2)"
0130f0f71fb0e831d18e6a3b33a3a50c,2,1,2,"List(PURCHASED:1, APPROVED:2)"
013e9c654a339d80b53513da3c1ea437,2,1,2,"List(PURCHASED:1, APPROVED:2)"
0148d3df00cebda592d4e5f966e300cc,2,1,2,"List(PURCHASED:1, APPROVED:2)"


In [0]:
%sql
SELECT
    order_id,
    customer_id,
    order_status,
    order_purchase_timestamp,
    order_approved_at,
    order_delivered_carrier_date,
    order_delivered_customer_date,
    order_estimated_delivery_date
FROM dev_customer360.silver.order_current
WHERE order_id = '0010dedd556712d7bb69a19cb7bbd37a';

order_id,customer_id,order_status,order_purchase_timestamp,order_approved_at,order_delivered_carrier_date,order_delivered_customer_date,order_estimated_delivery_date
0010dedd556712d7bb69a19cb7bbd37a,3a92efdb6e6163dc1734d44f2f5f6d04,approved,2017-10-21T19:32:06.000Z,2017-10-24T03:25:32.000Z,null,null,2017-11-03T00:00:00.000Z


In [0]:
from datetime import datetime
from uuid import uuid4

from pyspark.sql import Row

order_id = "0010dedd556712d7bb69a19cb7bbd37a"

source = (
    spark.table("dev_customer360.silver.order_current")
    .filter(f"order_id = '{order_id}'")
    .collect()
)

assert len(source) == 1

order = source[0]

assert order.order_status == "approved"
assert order.order_delivered_carrier_date is None
assert order.order_delivered_customer_date is None

shipping_time = datetime(2017, 10, 25, 10, 0, 0)
delivery_time = datetime(2017, 10, 29, 15, 0, 0)

assert order.order_approved_at < shipping_time < delivery_time
assert delivery_time < order.order_estimated_delivery_date

cdc_columns = [
    "order_id",
    "customer_id",
    "order_status",
    "order_purchase_timestamp",
    "order_approved_at",
    "order_delivered_carrier_date",
    "order_delivered_customer_date",
    "order_estimated_delivery_date",
    "_event_type",
    "_lifecycle_rank",
    "_event_timestamp",
    "_sequence_number",
    "_operation",
    "_change_id",
]

def create_order_event(status, sequence, event_time):
    return {
        "order_id": order.order_id,
        "customer_id": order.customer_id,
        "order_status": status,
        "order_purchase_timestamp": order.order_purchase_timestamp,
        "order_approved_at": order.order_approved_at,
        "order_delivered_carrier_date": shipping_time,
        "order_delivered_customer_date": (
            delivery_time if status == "delivered" else None
        ),
        "order_estimated_delivery_date": order.order_estimated_delivery_date,
        "_event_type": status.upper(),
        "_lifecycle_rank": sequence,
        "_event_timestamp": event_time,
        "_sequence_number": sequence,
        "_operation": "UPDATE",
        "_change_id": f"SIM_ORDER_{status.upper()}_{uuid4().hex}",
    }

shipped_event = create_order_event(
    "shipped", 3, shipping_time
)

delivered_event = create_order_event(
    "delivered", 4, delivery_time
)

events_df = spark.createDataFrame(
    [
        Row(**shipped_event),
        Row(**delivered_event),
    ]
).select(*cdc_columns)

display(
    events_df.select(
        "order_id",
        "order_status",
        "_event_type",
        "_sequence_number",
        "_event_timestamp",
        "order_delivered_carrier_date",
        "order_delivered_customer_date",
        "_change_id",
    ).orderBy("_sequence_number")
)

order_id,order_status,_event_type,_sequence_number,_event_timestamp,order_delivered_carrier_date,order_delivered_customer_date,_change_id
0010dedd556712d7bb69a19cb7bbd37a,shipped,SHIPPED,3,2017-10-25T10:00:00.000Z,2017-10-25T10:00:00.000Z,null,SIM_ORDER_SHIPPED_70daf78fd2534afb94cbf0706d0ed642
0010dedd556712d7bb69a19cb7bbd37a,delivered,DELIVERED,4,2017-10-29T15:00:00.000Z,2017-10-25T10:00:00.000Z,2017-10-29T15:00:00.000Z,SIM_ORDER_DELIVERED_91cac3e3a80b4ec68b86d08f06e4714f


In [0]:
from uuid import uuid4
from pyspark.sql import functions as F

# Select ONLY the DELIVERED event
delivered_df = events_df.filter(
    F.col("_sequence_number") == 4
)

assert delivered_df.count() == 1
assert delivered_df.first()["_event_type"] == "DELIVERED"

landing_path = (
    "/Volumes/dev_customer360/bronze/landing/"
    "cdc_simulator/orders"
)

batch_id = uuid4().hex

output_path = (
    f"{landing_path}/out_of_order_delivered_{batch_id}"
)

(
    delivered_df
    .coalesce(1)
    .write
    .mode("append")
    .option("header", "true")
    .option(
        "timestampFormat",
        "yyyy-MM-dd'T'HH:mm:ss.SSSXXX"
    )
    .csv(output_path)
)

print("DELIVERED event written successfully")
print("Output path:", output_path)
print("Sequence:", delivered_df.first()["_sequence_number"])
print("Change ID:", delivered_df.first()["_change_id"])

DELIVERED event written successfully
Output path: /Volumes/dev_customer360/bronze/landing/cdc_simulator/orders/out_of_order_delivered_14a39b617f3b46e58d4a4efa9a992ed5
Sequence: 4
Change ID: SIM_ORDER_DELIVERED_91cac3e3a80b4ec68b86d08f06e4714f


In [0]:
%sql
SELECT
    order_id,
    order_status,
    _event_type,
    _sequence_number,
    _change_id,
    _rescued_data
FROM dev_customer360.bronze.bronze_order_cdc_simulated
WHERE _change_id =
    'SIM_ORDER_DELIVERED_91cac3e3a80b4ec68b86d08f06e4714f';

order_id,order_status,_event_type,_sequence_number,_change_id,_rescued_data
0010dedd556712d7bb69a19cb7bbd37a,delivered,DELIVERED,4,SIM_ORDER_DELIVERED_91cac3e3a80b4ec68b86d08f06e4714f,null


In [0]:
%sql
SELECT
    order_id,
    order_status,
    order_delivered_carrier_date,
    order_delivered_customer_date,
    _event_type,
    _change_id
FROM dev_customer360.silver.order_current
WHERE order_id = '0010dedd556712d7bb69a19cb7bbd37a';

order_id,order_status,order_delivered_carrier_date,order_delivered_customer_date,_event_type,_change_id
0010dedd556712d7bb69a19cb7bbd37a,delivered,2017-10-25T10:00:00.000Z,2017-10-29T15:00:00.000Z,DELIVERED,SIM_ORDER_DELIVERED_91cac3e3a80b4ec68b86d08f06e4714f


In [0]:
%sql
SELECT
    order_status,
    _event_type,
    __START_AT,
    __END_AT
FROM dev_customer360.silver.order_history
WHERE order_id = '0010dedd556712d7bb69a19cb7bbd37a'
ORDER BY __START_AT;

order_status,_event_type,__START_AT,__END_AT
purchased,PURCHASED,1,2
approved,APPROVED,2,4
delivered,DELIVERED,4,null


In [0]:
from uuid import uuid4
from pyspark.sql import functions as F

# Select only the late-arriving SHIPPED event
shipped_df = events_df.filter(
    F.col("_sequence_number") == 3
)

assert shipped_df.count() == 1
assert shipped_df.first()["_event_type"] == "SHIPPED"

landing_path = (
    "/Volumes/dev_customer360/bronze/landing/"
    "cdc_simulator/orders"
)

batch_id = uuid4().hex

output_path = (
    f"{landing_path}/late_shipped_batch_{batch_id}"
)

(
    shipped_df
    .coalesce(1)
    .write
    .mode("append")
    .option("header", "true")
    .option(
        "timestampFormat",
        "yyyy-MM-dd'T'HH:mm:ss.SSSXXX"
    )
    .csv(output_path)
)

print("Late SHIPPED event written successfully")
print("Output path:", output_path)
print("Sequence:", shipped_df.first()["_sequence_number"])
print("Change ID:", shipped_df.first()["_change_id"])

Late SHIPPED event written successfully
Output path: /Volumes/dev_customer360/bronze/landing/cdc_simulator/orders/late_shipped_batch_5e00304d4a6041d4a1727800d88342a9
Sequence: 3
Change ID: SIM_ORDER_SHIPPED_70daf78fd2534afb94cbf0706d0ed642


In [0]:
%sql
SELECT
    order_id,
    order_status,
    _event_type,
    _sequence_number,
    _change_id,
    _rescued_data
FROM dev_customer360.bronze.bronze_order_cdc_simulated
WHERE _change_id =
    'SIM_ORDER_SHIPPED_70daf78fd2534afb94cbf0706d0ed642';

order_id,order_status,_event_type,_sequence_number,_change_id,_rescued_data
0010dedd556712d7bb69a19cb7bbd37a,shipped,SHIPPED,3,SIM_ORDER_SHIPPED_70daf78fd2534afb94cbf0706d0ed642,null


In [0]:
%sql
SELECT
    order_id,
    order_status,
    _event_type,
    _change_id,
    order_delivered_carrier_date,
    order_delivered_customer_date
FROM dev_customer360.silver.order_current
WHERE order_id = '0010dedd556712d7bb69a19cb7bbd37a';

order_id,order_status,_event_type,_change_id,order_delivered_carrier_date,order_delivered_customer_date
0010dedd556712d7bb69a19cb7bbd37a,delivered,DELIVERED,SIM_ORDER_DELIVERED_91cac3e3a80b4ec68b86d08f06e4714f,2017-10-25T10:00:00.000Z,2017-10-29T15:00:00.000Z


In [0]:
%sql
SELECT
    order_status,
    _event_type,
    __START_AT,
    __END_AT
FROM dev_customer360.silver.order_history
WHERE order_id = '0010dedd556712d7bb69a19cb7bbd37a'
ORDER BY __START_AT;

order_status,_event_type,__START_AT,__END_AT
purchased,PURCHASED,1,2
approved,APPROVED,2,3
shipped,SHIPPED,3,4
delivered,DELIVERED,4,null


In [0]:
%sql
SELECT
    'order_current' AS source_table,
    COUNT(*) AS matching_rows
FROM dev_customer360.silver.order_current
WHERE order_id = 'SIM_ORDER_DELETE_TEST_001'

UNION ALL

SELECT
    'order_history' AS source_table,
    COUNT(*) AS matching_rows
FROM dev_customer360.silver.order_history
WHERE order_id = 'SIM_ORDER_DELETE_TEST_001';

source_table,matching_rows
order_current,0
order_history,0


In [0]:
from pyspark.sql.types import (
    StructType,
    StructField,
    StringType,
    TimestampType,
    IntegerType,
    LongType
)

insert_schema = StructType([
    StructField("order_id", StringType(), True),
    StructField("customer_id", StringType(), True),
    StructField("order_status", StringType(), True),
    StructField("order_purchase_timestamp", TimestampType(), True),
    StructField("order_approved_at", TimestampType(), True),
    StructField("order_delivered_carrier_date", TimestampType(), True),
    StructField("order_delivered_customer_date", TimestampType(), True),
    StructField("order_estimated_delivery_date", TimestampType(), True),
    StructField("_event_type", StringType(), True),
    StructField("_lifecycle_rank", IntegerType(), True),
    StructField("_event_timestamp", TimestampType(), True),
    StructField("_sequence_number", LongType(), True),
    StructField("_operation", StringType(), True),
    StructField("_change_id", StringType(), True)
])

insert_df = spark.createDataFrame(
    [insert_event],
    schema=insert_schema
)

display(insert_df)

order_id,customer_id,order_status,order_purchase_timestamp,order_approved_at,order_delivered_carrier_date,order_delivered_customer_date,order_estimated_delivery_date,_event_type,_lifecycle_rank,_event_timestamp,_sequence_number,_operation,_change_id
SIM_ORDER_DELETE_TEST_001,3a92efdb6e6163dc1734d44f2f5f6d04,created,2026-10-10T08:00:00.000Z,null,null,null,2026-10-17T08:00:00.000Z,PURCHASED,1,2026-10-10T08:00:00.000Z,1,INSERT,SIM_ORDER_INSERT_400e81f39efd4be6b2fe927804f61f98


In [0]:
from uuid import uuid4

landing_path = (
    "/Volumes/dev_customer360/bronze/landing/"
    "cdc_simulator/orders"
)

output_path = (
    f"{landing_path}/delete_test_insert_{uuid4().hex}"
)

assert insert_df.count() == 1

assert insert_df.first()["_operation"] == "INSERT"
assert insert_df.first()["_sequence_number"] == 1

(
    insert_df
    .coalesce(1)
    .write
    .mode("append")
    .option("header", "true")
    .option(
        "timestampFormat",
        "yyyy-MM-dd'T'HH:mm:ss.SSSXXX"
    )
    .csv(output_path)
)

print("INSERT event written successfully")
print("Output path:", output_path)
print("Order ID:", insert_df.first()["order_id"])
print("Sequence:", insert_df.first()["_sequence_number"])
print("Change ID:", insert_df.first()["_change_id"])

INSERT event written successfully
Output path: /Volumes/dev_customer360/bronze/landing/cdc_simulator/orders/delete_test_insert_91b6ff364d3a46168f661a30ae9f6766
Order ID: SIM_ORDER_DELETE_TEST_001
Sequence: 1
Change ID: SIM_ORDER_INSERT_400e81f39efd4be6b2fe927804f61f98


In [0]:
%sql
SELECT
    order_id,
    order_status,
    _operation,
    _sequence_number,
    _change_id,
    _rescued_data
FROM dev_customer360.bronze.bronze_order_cdc_simulated
WHERE order_id = 'SIM_ORDER_DELETE_TEST_001';

order_id,order_status,_operation,_sequence_number,_change_id,_rescued_data
SIM_ORDER_DELETE_TEST_001,created,INSERT,1,SIM_ORDER_INSERT_400e81f39efd4be6b2fe927804f61f98,null


In [0]:
%sql
SELECT
    order_id,
    customer_id,
    order_status,
    _event_type,
    _change_id
FROM dev_customer360.silver.order_current
WHERE order_id = 'SIM_ORDER_DELETE_TEST_001';

order_id,customer_id,order_status,_event_type,_change_id
SIM_ORDER_DELETE_TEST_001,3a92efdb6e6163dc1734d44f2f5f6d04,created,PURCHASED,SIM_ORDER_INSERT_400e81f39efd4be6b2fe927804f61f98


In [0]:
%sql
SELECT
    order_id,
    order_status,
    _event_type,
    __START_AT,
    __END_AT
FROM dev_customer360.silver.order_history
WHERE order_id = 'SIM_ORDER_DELETE_TEST_001'
ORDER BY __START_AT;

order_id,order_status,_event_type,__START_AT,__END_AT
SIM_ORDER_DELETE_TEST_001,created,PURCHASED,1,null


In [0]:
from datetime import datetime, timedelta
from uuid import uuid4
from pyspark.sql import Row

# Reuse the original synthetic INSERT event
original = insert_df.first().asDict()

# Build DELETE event from the original record
delete_event = original.copy()

delete_event.update({
    "_operation": "DELETE",
    "_sequence_number": 2,
    "_event_type": "DELETED",
    "_event_timestamp": (
        original["_event_timestamp"] + timedelta(days=1)
    ),
    "_change_id": f"SIM_ORDER_DELETE_{uuid4().hex}"
})

# Use the existing explicit schema
delete_df = spark.createDataFrame(
    [delete_event],
    schema=insert_schema
)

assert delete_df.count() == 1
assert delete_df.first()["_operation"] == "DELETE"
assert delete_df.first()["_sequence_number"] == 2
assert delete_df.first()["order_id"] == "SIM_ORDER_DELETE_TEST_001"

display(
    delete_df.select(
        "order_id",
        "order_status",
        "_event_type",
        "_operation",
        "_sequence_number",
        "_event_timestamp",
        "_change_id"
    )
)

order_id,order_status,_event_type,_operation,_sequence_number,_event_timestamp,_change_id
SIM_ORDER_DELETE_TEST_001,created,DELETED,DELETE,2,2026-10-11T08:00:00.000Z,SIM_ORDER_DELETE_db81b57ea8cf4ba9bc8b534639681c1d


In [0]:
from uuid import uuid4

landing_path = (
    "/Volumes/dev_customer360/bronze/landing/"
    "cdc_simulator/orders"
)

output_path = (
    f"{landing_path}/delete_test_delete_{uuid4().hex}"
)

# Safety validations
assert delete_df.count() == 1

record = delete_df.first()

assert record["order_id"] == "SIM_ORDER_DELETE_TEST_001"
assert record["_operation"] == "DELETE"
assert record["_sequence_number"] == 2

# Write DELETE event
(
    delete_df
    .coalesce(1)
    .write
    .mode("append")
    .option("header", "true")
    .option(
        "timestampFormat",
        "yyyy-MM-dd'T'HH:mm:ss.SSSXXX"
    )
    .csv(output_path)
)

print("DELETE event written successfully")
print("Output path:", output_path)
print("Order ID:", record["order_id"])
print("Sequence:", record["_sequence_number"])
print("Change ID:", record["_change_id"])

DELETE event written successfully
Output path: /Volumes/dev_customer360/bronze/landing/cdc_simulator/orders/delete_test_delete_13e1d866bcd54c1bb7eb67835b383e8b
Order ID: SIM_ORDER_DELETE_TEST_001
Sequence: 2
Change ID: SIM_ORDER_DELETE_db81b57ea8cf4ba9bc8b534639681c1d


In [0]:
%sql
SELECT
    order_id,
    _operation,
    _event_type,
    _sequence_number,
    _change_id,
    _rescued_data
FROM dev_customer360.bronze.bronze_order_cdc_simulated
WHERE order_id = 'SIM_ORDER_DELETE_TEST_001'
ORDER BY _sequence_number;

order_id,_operation,_event_type,_sequence_number,_change_id,_rescued_data
SIM_ORDER_DELETE_TEST_001,INSERT,PURCHASED,1,SIM_ORDER_INSERT_400e81f39efd4be6b2fe927804f61f98,null
SIM_ORDER_DELETE_TEST_001,DELETE,DELETED,2,SIM_ORDER_DELETE_db81b57ea8cf4ba9bc8b534639681c1d,null


In [0]:
%sql
SELECT
    COUNT(*) AS current_order_count
FROM dev_customer360.silver.order_current
WHERE order_id = 'SIM_ORDER_DELETE_TEST_001';

current_order_count
0


In [0]:
%sql
SELECT
    order_id,
    order_status,
    _event_type,
    __START_AT,
    __END_AT
FROM dev_customer360.silver.order_history
WHERE order_id = 'SIM_ORDER_DELETE_TEST_001'
ORDER BY __START_AT;

order_id,order_status,_event_type,__START_AT,__END_AT
SIM_ORDER_DELETE_TEST_001,created,PURCHASED,1,2


In [0]:
%sql
SELECT
    'BRONZE_INSERT' AS validation,
    COUNT(*) AS actual_count
FROM dev_customer360.bronze.bronze_order_cdc_simulated
WHERE order_id = 'SIM_ORDER_DELETE_TEST_001'
  AND _operation = 'INSERT'

UNION ALL

SELECT
    'BRONZE_DELETE',
    COUNT(*)
FROM dev_customer360.bronze.bronze_order_cdc_simulated
WHERE order_id = 'SIM_ORDER_DELETE_TEST_001'
  AND _operation = 'DELETE'

UNION ALL

SELECT
    'SCD1_CURRENT',
    COUNT(*)
FROM dev_customer360.silver.order_current
WHERE order_id = 'SIM_ORDER_DELETE_TEST_001'

UNION ALL

SELECT
    'SCD2_ACTIVE',
    COUNT(*)
FROM dev_customer360.silver.order_history
WHERE order_id = 'SIM_ORDER_DELETE_TEST_001'
  AND __END_AT IS NULL;

validation,actual_count
BRONZE_INSERT,1
BRONZE_DELETE,1
SCD1_CURRENT,0
SCD2_ACTIVE,0


In [0]:
%sql
SELECT
    'CUSTOMERS' AS entity,
    (SELECT COUNT(*)
     FROM dev_customer360.silver.customer_current)
        AS current_rows,
    (SELECT COUNT(*)
     FROM dev_customer360.silver.customer_history
     WHERE __END_AT IS NULL)
        AS active_history_rows,
    (SELECT COUNT(*)
     FROM dev_customer360.silver.customer_history)
        AS total_history_rows

UNION ALL

SELECT
    'ORDERS' AS entity,
    (SELECT COUNT(*)
     FROM dev_customer360.silver.order_current),
    (SELECT COUNT(*)
     FROM dev_customer360.silver.order_history
     WHERE __END_AT IS NULL),
    (SELECT COUNT(*)
     FROM dev_customer360.silver.order_history);

entity,current_rows,active_history_rows,total_history_rows
CUSTOMERS,96096,96096,96358
ORDERS,99441,99441,392694


In [0]:
%sql
WITH validation AS (

    SELECT
        'CUSTOMER_SCD1_DUPLICATES' AS check_name,
        COUNT(*) AS issue_count
    FROM (
        SELECT customer_id
        FROM dev_customer360.silver.customer_current
        GROUP BY customer_id
        HAVING COUNT(*) > 1
    )

    UNION ALL

    SELECT
        'CUSTOMER_SCD2_MULTIPLE_ACTIVE',
        COUNT(*)
    FROM (
        SELECT customer_id
        FROM dev_customer360.silver.customer_history
        WHERE __END_AT IS NULL
        GROUP BY customer_id
        HAVING COUNT(*) > 1
    )

    UNION ALL

    SELECT
        'ORDER_SCD1_DUPLICATES',
        COUNT(*)
    FROM (
        SELECT order_id
        FROM dev_customer360.silver.order_current
        GROUP BY order_id
        HAVING COUNT(*) > 1
    )

    UNION ALL

    SELECT
        'ORDER_SCD2_MULTIPLE_ACTIVE',
        COUNT(*)
    FROM (
        SELECT order_id
        FROM dev_customer360.silver.order_history
        WHERE __END_AT IS NULL
        GROUP BY order_id
        HAVING COUNT(*) > 1
    )
)

SELECT *
FROM validation
ORDER BY check_name;

check_name,issue_count
CUSTOMER_SCD1_DUPLICATES,0
CUSTOMER_SCD2_MULTIPLE_ACTIVE,0
ORDER_SCD1_DUPLICATES,0
ORDER_SCD2_MULTIPLE_ACTIVE,0


In [0]:
%sql
WITH all_history AS (

    SELECT
        'CUSTOMERS' AS entity,
        customer_id AS business_key,
        __START_AT,
        __END_AT
    FROM dev_customer360.silver.customer_history

    UNION ALL

    SELECT
        'ORDERS' AS entity,
        order_id AS business_key,
        __START_AT,
        __END_AT
    FROM dev_customer360.silver.order_history
),

ordered_history AS (

    SELECT
        *,
        LEAD(__START_AT) OVER (
            PARTITION BY entity, business_key
            ORDER BY __START_AT
        ) AS next_start
    FROM all_history
)

SELECT
    entity,

    SUM(
        CASE
            WHEN __START_AT IS NULL
            THEN 1 ELSE 0
        END
    ) AS null_start_count,

    SUM(
        CASE
            WHEN __END_AT IS NOT NULL
             AND __END_AT <= __START_AT
            THEN 1 ELSE 0
        END
    ) AS invalid_interval_count,

    SUM(
        CASE
            WHEN next_start IS NOT NULL
             AND (
                 __END_AT IS NULL
                 OR __END_AT > next_start
             )
            THEN 1 ELSE 0
        END
    ) AS overlapping_interval_count

FROM ordered_history
GROUP BY entity
ORDER BY entity;

entity,null_start_count,invalid_interval_count,overlapping_interval_count
CUSTOMERS,0,0,0
ORDERS,0,0,0


In [0]:
spark.table(
    "dev_customer360.bronze.bronze_order_items"
).printSchema()

root
 |-- order_id: string (nullable = true)
 |-- order_item_id: integer (nullable = true)
 |-- product_id: string (nullable = true)
 |-- seller_id: string (nullable = true)
 |-- shipping_limit_date: timestamp (nullable = true)
 |-- price: double (nullable = true)
 |-- freight_value: double (nullable = true)
 |-- _rescued_data: string (nullable = true)
 |-- _source_system: string (nullable = true)
 |-- _source_entity: string (nullable = true)
 |-- _source_file_path: string (nullable = true)
 |-- _source_file_name: string (nullable = true)
 |-- _source_file_size: long (nullable = true)
 |-- _source_file_modification_time: timestamp (nullable = true)
 |-- _ingestion_timestamp: timestamp (nullable = true)
 |-- _ingestion_date: date (nullable = true)
 |-- _record_hash: string (nullable = true)



In [0]:
%sql
SELECT *
FROM dev_customer360.bronze.bronze_order_items
LIMIT 5;

order_id,order_item_id,product_id,seller_id,shipping_limit_date,price,freight_value,_rescued_data,_source_system,_source_entity,_source_file_path,_source_file_name,_source_file_size,_source_file_modification_time,_ingestion_timestamp,_ingestion_date,_record_hash
b5b967cc29ff5ce57bb11ffd9c2e9101,1,7b85e3deef35afd6ebed5461ee8f0641,ede0c03645598cdfc63ca8237acbe73d,2018-03-07T00:10:25.000Z,30.21,15.1,null,olist,order_items,/Volumes/dev_customer360/bronze/landing/olist/order_items/olist_order_items_dataset.csv,olist_order_items_dataset.csv,15438671,2026-10-02T13:06:56.000Z,2026-10-02T13:26:39.056Z,2026-10-02,c3d52e74028d67d72cb529cbcf26d5ad8f5f2283a734ccbe3e55047c9f3b6e9b
b5b9c285b121f832e405d1de17e9db46,1,629e019a6f298a83aeecc7877964f935,c003204e1ab016dfa150abc119207b24,2018-08-13T15:05:13.000Z,107.9,23.56,null,olist,order_items,/Volumes/dev_customer360/bronze/landing/olist/order_items/olist_order_items_dataset.csv,olist_order_items_dataset.csv,15438671,2026-10-02T13:06:56.000Z,2026-10-02T13:26:39.056Z,2026-10-02,5d959d2f03ed73993940bb3b00545827c2409d7afaa7981531c8c698afaeae7e
b5ba129c3461e787bf826b827b5a03ab,1,5fc604f5f76a23b94565f06a830fa835,cee48807215b30a12ca2ca10ffb5f250,2017-10-26T13:14:51.000Z,111.9,15.53,null,olist,order_items,/Volumes/dev_customer360/bronze/landing/olist/order_items/olist_order_items_dataset.csv,olist_order_items_dataset.csv,15438671,2026-10-02T13:06:56.000Z,2026-10-02T13:26:39.056Z,2026-10-02,08395d23792f000e6dba569c3435350b68d428b896b47922d83bcd9bb159f7d2
b5bbf794f21db63d343d4e0ec7f9194a,1,b7a89537c40b1f5a18b5ba75dbb91cbe,7b0df942f46435babab05d49b744b2c4,2017-04-26T21:35:21.000Z,278.77,13.34,null,olist,order_items,/Volumes/dev_customer360/bronze/landing/olist/order_items/olist_order_items_dataset.csv,olist_order_items_dataset.csv,15438671,2026-10-02T13:06:56.000Z,2026-10-02T13:26:39.056Z,2026-10-02,c6898ccf59911b6ee296790f82c2c2df2c1598201ad12fca9b355e014ea2b9d4
b5bccf69e002eae737904e21c79ad3e6,1,3c0c5eee30aef7a844410f1d1397b620,701938c450705b8ae65fc923b70f35c7,2018-02-05T17:58:02.000Z,109.97,45.23,null,olist,order_items,/Volumes/dev_customer360/bronze/landing/olist/order_items/olist_order_items_dataset.csv,olist_order_items_dataset.csv,15438671,2026-10-02T13:06:56.000Z,2026-10-02T13:26:39.056Z,2026-10-02,99d37866895c768eb56094f4a61055a04a7fbe568eff78b2b68b6aa12725be57


In [0]:
%sql
SELECT
    COUNT(*) AS total_rows,

    COUNT_IF(order_id IS NULL) AS null_order_id,
    COUNT_IF(order_item_id IS NULL) AS null_order_item_id,
    COUNT_IF(product_id IS NULL) AS null_product_id,
    COUNT_IF(seller_id IS NULL) AS null_seller_id,

    COUNT_IF(shipping_limit_date IS NULL)
        AS null_shipping_limit_date,

    COUNT_IF(price IS NULL) AS null_price,
    COUNT_IF(freight_value IS NULL) AS null_freight_value,

    COUNT_IF(price <= 0) AS invalid_price,
    COUNT_IF(freight_value < 0) AS negative_freight,

    COUNT_IF(_rescued_data IS NOT NULL) AS rescued_rows,

    COUNT(DISTINCT struct(order_id, order_item_id))
        AS distinct_business_keys

FROM dev_customer360.bronze.bronze_order_items;

total_rows,null_order_id,null_order_item_id,null_product_id,null_seller_id,null_shipping_limit_date,null_price,null_freight_value,invalid_price,negative_freight,rescued_rows,distinct_business_keys
112650,0,0,0,0,0,0,0,0,0,0,112650


In [0]:
%sql
SELECT
    COUNT(*) AS total_order_items,

    COUNT_IF(o.order_id IS NULL)
        AS missing_order_references,

    COUNT_IF(p.product_id IS NULL)
        AS missing_product_references,

    COUNT_IF(s.seller_id IS NULL)
        AS missing_seller_references

FROM dev_customer360.bronze.bronze_order_items i

LEFT JOIN dev_customer360.silver.order_current o
    ON i.order_id = o.order_id

LEFT JOIN dev_customer360.bronze.bronze_products p
    ON i.product_id = p.product_id

LEFT JOIN dev_customer360.bronze.bronze_sellers s
    ON i.seller_id = s.seller_id;

total_order_items,missing_order_references,missing_product_references,missing_seller_references
112650,0,0,0


In [0]:
%sql
SELECT
    'BRONZE' AS layer,
    COUNT(*) AS total_rows,
    COUNT(DISTINCT STRUCT(order_id, order_item_id))
        AS distinct_business_keys
FROM dev_customer360.bronze.bronze_order_items

UNION ALL

SELECT
    'SILVER' AS layer,
    COUNT(*) AS total_rows,
    COUNT(DISTINCT STRUCT(order_id, order_item_id))
        AS distinct_business_keys
FROM dev_customer360.silver.order_items;

layer,total_rows,distinct_business_keys
BRONZE,112650,112650
SILVER,112650,112650


In [0]:
%sql
DESCRIBE TABLE dev_customer360.silver.order_items;

col_name,data_type,comment
order_id,string,null
order_item_id,int,null
product_id,string,null
seller_id,string,null
shipping_limit_date,timestamp,null
price,"decimal(18,2)",null
freight_value,"decimal(18,2)",null
_record_hash,string,null
_source_system,string,null
_source_file_path,string,null


In [0]:
%sql
WITH counts AS (
    SELECT
        (SELECT COUNT(*)
         FROM dev_customer360.bronze.bronze_order_items)
            AS bronze_rows,

        (SELECT COUNT(*)
         FROM dev_customer360.silver.order_items)
            AS silver_rows,

        (SELECT COUNT(*)
         FROM dev_customer360.silver.order_items_quarantine)
            AS quarantine_rows
)

SELECT
    bronze_rows,
    silver_rows,
    quarantine_rows,
    silver_rows + quarantine_rows AS accounted_rows,
    bronze_rows - silver_rows - quarantine_rows
        AS reconciliation_difference
FROM counts;

bronze_rows,silver_rows,quarantine_rows,accounted_rows,reconciliation_difference
112650,112650,0,112650,0


In [0]:
from pyspark.sql import functions as F

bronze_df = spark.table(
    "dev_customer360.bronze.bronze_order_items"
)

# Reuse an existing row to preserve the correct schema
sample_df = bronze_df.limit(1)

invalid_df = (
    sample_df
    .withColumn(
        "order_id",
        F.lit("SIM_INVALID_ORDER_ITEM_001")
    )
    .withColumn(
        "order_item_id",
        F.lit(1)
    )
    .withColumn(
        "price",
        F.lit(-100.00)
    )
    .withColumn(
        "freight_value",
        F.lit(15.00)
    )
)

display(
    invalid_df.select(
        "order_id",
        "order_item_id",
        "price",
        "freight_value",
        "_rescued_data"
    )
)

order_id,order_item_id,price,freight_value,_rescued_data
SIM_INVALID_ORDER_ITEM_001,1,-100.0,15.0,null


In [0]:
import os
import sys

print("Current directory:", os.getcwd())
print("Python search paths:")
for path in sys.path:
    print(path)

Current directory: /Workspace/Users/karayatprabhakar@gmail.com/customer360/setup
Python search paths:
/databricks/python_shell/scripts
/databricks/spark/python/lib/py4j-0.10.9.9-src.zip
/databricks/python_shell/lib
/usr/lib/python312.zip
/usr/lib/python3.12
/usr/lib/python3.12/lib-dynload
/local_disk0/.ephemeral_nfs/envs/pythonEnv-da9af5a9-97aa-45c1-81e1-d18d09afceae/lib/python3.12/site-packages
/databricks/python/lib/python3.12/site-packages
/usr/local/lib/python3.12/dist-packages
/usr/lib/python3/dist-packages

/Workspace/Users/karayatprabhakar@gmail.com/customer360/setup


In [0]:
import os

workspace_root = "/Workspace"

for root, dirs, files in os.walk(workspace_root):
    if "order_items_validator.py" in files:
        print("Validator found:", os.path.join(root, "order_items_validator.py"))
        break

Validator found: /Workspace/Users/karayatprabhakar@gmail.com/customer360_lakeflow_pipeline/framework/order_items_validator.py


In [0]:
import sys

# Replace with the actual workspace path.
project_root = "/Workspace/Users/karayatprabhakar@gmail.com/customer360_lakeflow_pipeline"

if project_root not in sys.path:
    sys.path.insert(0, project_root)

from framework.order_items_validator import OrderItemsValidator

print("Validator imported successfully")

Validator imported successfully


In [0]:
import traceback

print("Step 1: Checking input DataFrame")
invalid_df.printSchema()

print("\nStep 2: Applying validator")

try:
    validated_df = OrderItemsValidator.validate(invalid_df)

    print("Validator transformation created successfully")

    print("\nStep 3: Displaying validation result")

    display(
        validated_df.select(
            "order_id",
            "price",
            "_dq_errors"
        )
    )

    print("\nStep 4: Checking rejection reasons")

    result = validated_df.first()

    print("Actual errors:", result["_dq_errors"])
    print("Expected errors:", ["INVALID_PRICE"])

    assert result["_dq_errors"] == ["INVALID_PRICE"]

    print("PASS: Invalid price correctly detected")

except Exception:
    traceback.print_exc()

Step 1: Checking input DataFrame


---------------------------------------------------------------------------
NameError                                 Traceback (most recent call last)
File <command-8583013144810080>, line 4
      1 import traceback
      3 print("Step 1: Checking input DataFrame")
----> 4 invalid_df.printSchema()
      6 print("\nStep 2: Applying validator")
      8 try:

NameError: name 'invalid_df' is not defined

In [0]:
from pyspark.sql import functions as F
from framework.order_items_validator import OrderItemsValidator

# 1. Read an existing Bronze record
bronze_df = spark.table(
    "dev_customer360.bronze.bronze_order_items"
)

# 2. Recreate the synthetic invalid record
invalid_df = (
    bronze_df.limit(1)
    .withColumn(
        "order_id",
        F.lit("SIM_INVALID_ORDER_ITEM_001")
    )
    .withColumn(
        "order_item_id",
        F.lit(1)
    )
    .withColumn(
        "price",
        F.lit(-100.00)
    )
    .withColumn(
        "freight_value",
        F.lit(15.00)
    )
)

# 3. Apply our shared validator
validated_df = OrderItemsValidator.validate(invalid_df)

# 4. Display validation results
display(
    validated_df.select(
        "order_id",
        "price",
        "freight_value",
        "_dq_errors"
    )
)

# 5. Automated assertion
result = validated_df.first()

assert result["_dq_errors"] == ["INVALID_PRICE"]

print("PASS: Invalid price correctly detected")

order_id,price,freight_value,_dq_errors
SIM_INVALID_ORDER_ITEM_001,-100.0,15.0,List(INVALID_PRICE)


PASS: Invalid price correctly detected


In [0]:
%sql
SELECT
    'BRONZE' AS layer,
    COUNT(*) AS matching_rows
FROM dev_customer360.bronze.bronze_order_items
WHERE order_id = 'SIM_INVALID_ORDER_ITEM_001'
  AND order_item_id = 1

UNION ALL

SELECT
    'SILVER',
    COUNT(*)
FROM dev_customer360.silver.order_items
WHERE order_id = 'SIM_INVALID_ORDER_ITEM_001'
  AND order_item_id = 1

UNION ALL

SELECT
    'QUARANTINE',
    COUNT(*)
FROM dev_customer360.silver.order_items_quarantine
WHERE order_id = 'SIM_INVALID_ORDER_ITEM_001'
  AND order_item_id = 1;

layer,matching_rows
BRONZE,0
SILVER,0
QUARANTINE,0


In [0]:
from uuid import uuid4

# Original Olist source contains seven business columns.
source_columns = [
    "order_id",
    "order_item_id",
    "product_id",
    "seller_id",
    "shipping_limit_date",
    "price",
    "freight_value"
]

test_df = invalid_df.select(*source_columns)

# Validate the record before writing.
assert test_df.count() == 1

record = test_df.first()

assert record["order_id"] == "SIM_INVALID_ORDER_ITEM_001"
assert record["order_item_id"] == 1
assert record["price"] == -100.0

# Match the existing Olist order_items landing structure.
landing_path = (
    "/Volumes/dev_customer360/bronze/landing/"
    "olist/order_items"
)

output_path = (
    f"{landing_path}/quarantine_test_{uuid4().hex}"
)

(
    test_df
    .coalesce(1)
    .write
    .mode("append")
    .option("header", "true")
    .option(
        "timestampFormat",
        "yyyy-MM-dd'T'HH:mm:ss.SSSXXX"
    )
    .csv(output_path)
)

print("Invalid order-item CSV written successfully")
print("Output path:", output_path)
print("Order ID:", record["order_id"])
print("Invalid price:", record["price"])

Invalid order-item CSV written successfully
Output path: /Volumes/dev_customer360/bronze/landing/olist/order_items/quarantine_test_610fe534bff147a8a5412d0e045ce8cf
Order ID: SIM_INVALID_ORDER_ITEM_001
Invalid price: -100.0


In [0]:
%sql
WITH counts AS (
    SELECT
        (SELECT COUNT(*)
         FROM dev_customer360.bronze.bronze_order_items)
            AS bronze_rows,

        (SELECT COUNT(*)
         FROM dev_customer360.silver.order_items)
            AS silver_rows,

        (SELECT COUNT(*)
         FROM dev_customer360.silver.order_items_quarantine)
            AS quarantine_rows
)

SELECT
    bronze_rows,
    silver_rows,
    quarantine_rows,
    silver_rows + quarantine_rows AS accounted_rows,
    bronze_rows - silver_rows - quarantine_rows
        AS reconciliation_difference
FROM counts;

bronze_rows,silver_rows,quarantine_rows,accounted_rows,reconciliation_difference
112651,112650,1,112651,0


In [0]:
%sql
SELECT
    order_id,
    order_item_id,
    price,
    freight_value,
    _dq_errors,
    _source_file_path
FROM dev_customer360.silver.order_items_quarantine
WHERE order_id = 'SIM_INVALID_ORDER_ITEM_001';

order_id,order_item_id,price,freight_value,_dq_errors,_source_file_path
SIM_INVALID_ORDER_ITEM_001,1,-100.0,15.0,List(INVALID_PRICE),/Volumes/dev_customer360/bronze/landing/olist/order_items/quarantine_test_610fe534bff147a8a5412d0e045ce8cf/part-00000-tid-7367124985399285614-c70b9d11-0f97-4db1-a6ef-91011347ba16-409-1-c000.csv


In [0]:
%sql
SELECT COUNT(*) AS invalid_records_in_silver
FROM dev_customer360.silver.order_items
WHERE order_id = 'SIM_INVALID_ORDER_ITEM_001';

invalid_records_in_silver
0


In [0]:
%sql
SELECT
    order_id,
    order_item_id,
    COUNT(*) AS occurrence_count,
    COUNT(DISTINCT _record_hash) AS distinct_record_versions
FROM dev_customer360.bronze.bronze_order_items
GROUP BY
    order_id,
    order_item_id
HAVING COUNT(*) > 1
ORDER BY occurrence_count DESC;

order_id,order_item_id,occurrence_count,distinct_record_versions


In [0]:
from pyspark.sql import functions as F

# Read one existing valid Bronze order item
base_df = (
    spark.table("dev_customer360.bronze.bronze_order_items")
    .filter(F.col("price") > 0)
    .limit(1)
)

# Original record
original_df = base_df

# Exact duplicate
exact_duplicate_df = base_df

# Conflicting duplicate: same key, different price
conflicting_duplicate_df = (
    base_df
    .withColumn("price", F.col("price") + F.lit(50.00))
)

# Combine all three records
test_df = (
    original_df
    .unionByName(exact_duplicate_df)
    .unionByName(conflicting_duplicate_df)
)

display(
    test_df.groupBy("order_id", "order_item_id")
    .agg(
        F.count("*").alias("occurrence_count"),
        F.countDistinct("price").alias("distinct_prices")
    )
)

order_id,order_item_id,occurrence_count,distinct_prices
b5b967cc29ff5ce57bb11ffd9c2e9101,1,3,2


In [0]:
from pyspark.sql import functions as F

business_key = ["order_id", "order_item_id"]

business_columns = [
    "order_id",
    "order_item_id",
    "product_id",
    "seller_id",
    "shipping_limit_date",
    "price",
    "freight_value"
]

# Remove identical business records for classification
distinct_records = test_df.select(*business_columns).distinct()

# Count all incoming records and distinct business versions
total_counts = (
    test_df
    .groupBy(*business_key)
    .agg(F.count("*").alias("total_records"))
)

version_counts = (
    distinct_records
    .groupBy(*business_key)
    .agg(F.count("*").alias("distinct_versions"))
)

classification_df = (
    total_counts
    .join(version_counts, business_key)
    .withColumn(
        "duplicate_status",
        F.when(
            F.col("distinct_versions") > 1,
            F.lit("CONFLICTING_DUPLICATE")
        )
        .when(
            F.col("total_records") > 1,
            F.lit("EXACT_DUPLICATE")
        )
        .otherwise(F.lit("UNIQUE"))
    )
)

display(classification_df)

order_id,order_item_id,total_records,distinct_versions,duplicate_status
b5b967cc29ff5ce57bb11ffd9c2e9101,1,3,2,CONFLICTING_DUPLICATE


In [0]:
from framework.order_items_deduplicator import OrderItemsDeduplicator

classified_df = OrderItemsDeduplicator.classify(test_df)

display(classified_df)

result = classified_df.first()

assert result["total_records"] == 3
assert result["distinct_versions"] == 2
assert result["duplicate_status"] == "CONFLICTING_DUPLICATE"

print("PASS: Reusable duplicate classifier works correctly")

order_id,order_item_id,total_records,distinct_versions,duplicate_status
b5b967cc29ff5ce57bb11ffd9c2e9101,1,3,2,CONFLICTING_DUPLICATE


PASS: Reusable duplicate classifier works correctly


In [0]:
from pyspark.sql import functions as F
from framework.order_items_deduplicator import OrderItemsDeduplicator

# Use the existing three-record test dataset.
original = test_df.limit(1)

# Create independent business keys for each scenario.
unique_df = original.withColumn(
    "order_id", F.lit("SIM_UNIQUE_001")
)

exact_df = (
    original
    .withColumn("order_id", F.lit("SIM_EXACT_001"))
)

conflict_df = (
    original
    .withColumn("order_id", F.lit("SIM_CONFLICT_001"))
)

# Assemble all scenarios.
all_tests_df = (
    unique_df
    .unionByName(exact_df)
    .unionByName(exact_df)
    .unionByName(conflict_df)
    .unionByName(
        conflict_df.withColumn(
            "price", F.col("price") + F.lit(50)
        )
    )
)

results_df = OrderItemsDeduplicator.classify(all_tests_df)

display(
    results_df.select(
        "order_id",
        "total_records",
        "distinct_versions",
        "duplicate_status"
    ).orderBy("order_id")
)

# Assertions
actual = {
    row["order_id"]: row["duplicate_status"]
    for row in results_df.collect()
}

assert actual["SIM_UNIQUE_001"] == "UNIQUE"
assert actual["SIM_EXACT_001"] == "EXACT_DUPLICATE"
assert actual["SIM_CONFLICT_001"] == "CONFLICTING_DUPLICATE"

print("PASS: All three duplicate classification scenarios")

order_id,total_records,distinct_versions,duplicate_status
SIM_CONFLICT_001,2,2,CONFLICTING_DUPLICATE
SIM_EXACT_001,2,1,EXACT_DUPLICATE
SIM_UNIQUE_001,1,1,UNIQUE


PASS: All three duplicate classification scenarios


In [0]:
import importlib
import framework.order_items_deduplicator as dedup_module

importlib.reload(dedup_module)

OrderItemsDeduplicator = dedup_module.OrderItemsDeduplicator

In [0]:
from framework.order_items_validator import OrderItemsValidator
from pyspark.sql import functions as F

# all_tests_df contains:
# 1 unique record
# 2 identical records
# 2 conflicting records

validated_test_df = OrderItemsValidator.validate(all_tests_df)

valid_df, quarantine_df = OrderItemsDeduplicator.route(
    validated_test_df
)

print("Input records:", validated_test_df.count())
print("Accepted records:", valid_df.count())
print("Quarantined records:", quarantine_df.count())

print("\nAccepted records:")
display(
    valid_df.select(
        "order_id",
        "order_item_id",
        "price",
        "duplicate_status"
    ).orderBy("order_id")
)

print("\nQuarantined records:")
display(
    quarantine_df.select(
        "order_id",
        "order_item_id",
        "price",
        "duplicate_status",
        "_dq_errors"
    ).orderBy("order_id")
)

# Automated assertions
assert validated_test_df.count() == 5
assert valid_df.count() == 2
assert quarantine_df.count() == 2

assert (
    valid_df.filter(
        F.col("order_id") == "SIM_EXACT_001"
    ).count() == 1
)

assert (
    quarantine_df.filter(
        F.col("order_id") == "SIM_CONFLICT_001"
    ).count() == 2
)

assert (
    quarantine_df.filter(
        F.array_contains(
            F.col("_dq_errors"),
            "CONFLICTING_DUPLICATE"
        )
    ).count() == 2
)

print("PASS: Duplicate routing test completed")

Input records: 5
Accepted records: 2
Quarantined records: 2

Accepted records:


order_id,order_item_id,price,duplicate_status
SIM_EXACT_001,1,30.21,EXACT_DUPLICATE
SIM_UNIQUE_001,1,30.21,UNIQUE



Quarantined records:


order_id,order_item_id,price,duplicate_status,_dq_errors
SIM_CONFLICT_001,1,30.21,CONFLICTING_DUPLICATE,List(CONFLICTING_DUPLICATE)
SIM_CONFLICT_001,1,80.21000000000001,CONFLICTING_DUPLICATE,List(CONFLICTING_DUPLICATE)


PASS: Duplicate routing test completed


In [0]:
import importlib
from pyspark.sql import functions as F

import framework.order_items_deduplicator as dedup_module

# Reload the latest framework code
importlib.reload(dedup_module)

OrderItemsDeduplicator = dedup_module.OrderItemsDeduplicator

from framework.order_items_validator import OrderItemsValidator

# 1. Get a valid Bronze record
base_df = (
    spark.table("dev_customer360.bronze.bronze_order_items")
    .filter(F.col("price") > 0)
    .limit(1)
)

# 2. Create a valid record
valid_test_df = (
    base_df
    .withColumn("order_id", F.lit("SIM_DQ_PRECEDENCE_001"))
    .withColumn("order_item_id", F.lit(1))
    .withColumn("price", F.lit(100.00))
)

# 3. Create an invalid record with the SAME business key
invalid_test_df = (
    valid_test_df
    .withColumn("price", F.lit(-100.00))
)

# 4. Combine both records
test_input_df = valid_test_df.unionByName(invalid_test_df)

# 5. Apply row-level validation
validated_df = OrderItemsValidator.validate(test_input_df)

# 6. Apply duplicate routing
accepted_df, quarantine_df = OrderItemsDeduplicator.route(
    validated_df
)

print("Input records:", test_input_df.count())
print("Accepted records:", accepted_df.count())
print("Quarantined records:", quarantine_df.count())

print("\nAccepted:")
display(
    accepted_df.select(
        "order_id",
        "price",
        "duplicate_status",
        "_dq_errors"
    )
)

print("\nQuarantine:")
display(
    quarantine_df.select(
        "order_id",
        "price",
        "_dq_errors"
    )
)

# 7. Automated assertions
assert test_input_df.count() == 2
assert accepted_df.count() == 1
assert quarantine_df.count() == 1

assert accepted_df.first()["price"] == 100.00

assert accepted_df.first()["duplicate_status"] == "UNIQUE"

assert quarantine_df.first()["_dq_errors"] == ["INVALID_PRICE"]

print("PASS: Validation precedence works correctly")

Input records: 2
Accepted records: 1
Quarantined records: 1

Accepted:


order_id,price,duplicate_status,_dq_errors
SIM_DQ_PRECEDENCE_001,100.0,UNIQUE,List()



Quarantine:


order_id,price,_dq_errors
SIM_DQ_PRECEDENCE_001,-100.0,List(INVALID_PRICE)


PASS: Validation precedence works correctly


In [0]:
import importlib
import framework.order_items_deduplicator as dedup_module

importlib.reload(dedup_module)

OrderItemsDeduplicator = dedup_module.OrderItemsDeduplicator

print("Updated deduplicator loaded successfully")

Updated deduplicator loaded successfully


In [0]:
from pyspark.sql import functions as F
from framework.order_items_validator import OrderItemsValidator

# 1. Select one valid Bronze record
base_df = (
    spark.table("dev_customer360.bronze.bronze_order_items")
    .filter(F.col("price") > 0)
    .limit(1)
)

# 2. Create earlier-ingested record
early_df = (
    base_df
    .withColumn("order_id", F.lit("SIM_SURVIVOR_TEST_001"))
    .withColumn(
        "_ingestion_timestamp",
        F.to_timestamp(F.lit("2026-10-01 10:00:00"))
    )
    .withColumn(
        "_source_file_path",
        F.lit("/test/batch_early.csv")
    )
    .withColumn(
        "_source_file_name",
        F.lit("batch_early.csv")
    )
)

# 3. Create later-ingested record
late_df = (
    early_df
    .withColumn(
        "_ingestion_timestamp",
        F.to_timestamp(F.lit("2026-10-02 10:00:00"))
    )
    .withColumn(
        "_source_file_path",
        F.lit("/test/batch_late.csv")
    )
    .withColumn(
        "_source_file_name",
        F.lit("batch_late.csv")
    )
)

# 4. Combine and validate
test_df = early_df.unionByName(late_df)

validated_df = OrderItemsValidator.validate(test_df)

# 5. Apply deduplication routing
accepted_df, quarantine_df = OrderItemsDeduplicator.route(
    validated_df
)

# 6. Display results
display(
    accepted_df.select(
        "order_id",
        "duplicate_status",
        "_ingestion_timestamp",
        "_source_file_path"
    )
)

# 7. Assertions
assert test_df.count() == 2
assert accepted_df.count() == 1
assert quarantine_df.count() == 0

survivor = accepted_df.first()

assert survivor["duplicate_status"] == "EXACT_DUPLICATE"
assert survivor["_source_file_path"] == "/test/batch_early.csv"

print("PASS: Earliest-ingested exact duplicate selected")

order_id,duplicate_status,_ingestion_timestamp,_source_file_path
SIM_SURVIVOR_TEST_001,EXACT_DUPLICATE,2026-10-01T10:00:00.000Z,/test/batch_early.csv


PASS: Earliest-ingested exact duplicate selected


In [0]:
%sql
WITH counts AS (
    SELECT
        (SELECT COUNT(*)
         FROM dev_customer360.bronze.bronze_order_items)
            AS bronze_rows,

        (SELECT COUNT(*)
         FROM dev_customer360.silver.order_items)
            AS silver_rows,

        (SELECT COUNT(*)
         FROM dev_customer360.silver.order_items_quarantine)
            AS quarantine_rows,

        (SELECT COUNT(*)
         FROM dev_customer360.silver.order_items_duplicates_audit)
            AS suppressed_duplicates
)

SELECT
    bronze_rows,
    silver_rows,
    quarantine_rows,
    suppressed_duplicates,

    silver_rows
        + quarantine_rows
        + suppressed_duplicates AS accounted_rows,

    bronze_rows
        - silver_rows
        - quarantine_rows
        - suppressed_duplicates AS reconciliation_difference
FROM counts;

bronze_rows,silver_rows,quarantine_rows,suppressed_duplicates,accounted_rows,reconciliation_difference
112651,112650,1,0,112651,0


In [0]:
from pyspark.sql import functions as F

source_columns = [
    "order_id",
    "order_item_id",
    "product_id",
    "seller_id",
    "shipping_limit_date",
    "price",
    "freight_value"
]

# Select an existing valid order item.
duplicate_df = (
    spark.table("dev_customer360.bronze.bronze_order_items")
    .filter(
        (F.col("price") > 0) &
        (F.col("order_id") != "SIM_INVALID_ORDER_ITEM_001")
    )
    .orderBy("order_id", "order_item_id")
    .limit(1)
    .select(*source_columns)
)

display(duplicate_df)

order_id,order_item_id,product_id,seller_id,shipping_limit_date,price,freight_value
00010242fe8c5a6d1ba2dd792cb16214,1,4244733e06e7ecb4970a6e2683c13e61,48436dade18ac8b2bce089ec2a041202,2017-09-19T09:45:35.000Z,58.9,13.29


In [0]:
%sql
SELECT
    'BRONZE' AS layer,
    COUNT(*) AS record_count
FROM dev_customer360.bronze.bronze_order_items
WHERE order_id = '00010242fe8c5a6d1ba2dd792cb16214'
  AND order_item_id = 1

UNION ALL

SELECT
    'SILVER',
    COUNT(*)
FROM dev_customer360.silver.order_items
WHERE order_id = '00010242fe8c5a6d1ba2dd792cb16214'
  AND order_item_id = 1

UNION ALL

SELECT
    'DUPLICATE_AUDIT',
    COUNT(*)
FROM dev_customer360.silver.order_items_duplicates_audit
WHERE order_id = '00010242fe8c5a6d1ba2dd792cb16214'
  AND order_item_id = 1

UNION ALL

SELECT
    'QUARANTINE',
    COUNT(*)
FROM dev_customer360.silver.order_items_quarantine
WHERE order_id = '00010242fe8c5a6d1ba2dd792cb16214'
  AND order_item_id = 1;

layer,record_count
BRONZE,1
SILVER,1
DUPLICATE_AUDIT,0
QUARANTINE,0


In [0]:
from uuid import uuid4
from pyspark.sql import functions as F

# Original seven Olist business columns
source_columns = [
    "order_id",
    "order_item_id",
    "product_id",
    "seller_id",
    "shipping_limit_date",
    "price",
    "freight_value"
]

# Recreate the source record from Bronze so the
# test works even if notebook variables were cleared.
duplicate_df = (
    spark.table("dev_customer360.bronze.bronze_order_items")
    .filter(
        (F.col("order_id") ==
         "00010242fe8c5a6d1ba2dd792cb16214") &
        (F.col("order_item_id") == 1)
    )
    .select(*source_columns)
)

# Safety checks
assert duplicate_df.count() == 1

record = duplicate_df.first()

assert float(record["price"]) == 58.90
assert float(record["freight_value"]) == 13.29

# Existing Auto Loader landing directory
landing_path = (
    "/Volumes/dev_customer360/bronze/landing/"
    "olist/order_items"
)

# Unique test batch folder
output_path = (
    f"{landing_path}/"
    f"exact_duplicate_test_{uuid4().hex}"
)

# Write one new CSV file.
(
    duplicate_df
    .coalesce(1)
    .write
    .mode("append")
    .option("header", "true")
    .option(
        "timestampFormat",
        "yyyy-MM-dd'T'HH:mm:ss.SSSXXX"
    )
    .csv(output_path)
)

print("PASS: Exact duplicate CSV created")
print("Output path:", output_path)
print("Order ID:", record["order_id"])
print("Order Item ID:", record["order_item_id"])
print("Price:", record["price"])

PASS: Exact duplicate CSV created
Output path: /Volumes/dev_customer360/bronze/landing/olist/order_items/exact_duplicate_test_e71d908b5e984a4dbc34e0e8471d3356
Order ID: 00010242fe8c5a6d1ba2dd792cb16214
Order Item ID: 1
Price: 58.9


In [0]:
%sql
WITH counts AS (
    SELECT
        (SELECT COUNT(*)
         FROM dev_customer360.bronze.bronze_order_items)
            AS bronze_rows,

        (SELECT COUNT(*)
         FROM dev_customer360.silver.order_items)
            AS silver_rows,

        (SELECT COUNT(*)
         FROM dev_customer360.silver.order_items_quarantine)
            AS quarantine_rows,

        (SELECT COUNT(*)
         FROM dev_customer360.silver.order_items_duplicates_audit)
            AS suppressed_duplicates
)

SELECT
    bronze_rows,
    silver_rows,
    quarantine_rows,
    suppressed_duplicates,

    silver_rows + quarantine_rows + suppressed_duplicates
        AS accounted_rows,

    bronze_rows - silver_rows - quarantine_rows
        - suppressed_duplicates AS reconciliation_difference
FROM counts;

bronze_rows,silver_rows,quarantine_rows,suppressed_duplicates,accounted_rows,reconciliation_difference
112652,112650,1,1,112652,0


In [0]:
%sql
SELECT
    order_id,
    order_item_id,
    price,
    duplicate_status,
    _source_file_path,
    _ingestion_timestamp
FROM dev_customer360.silver.order_items_duplicates_audit
WHERE order_id = '00010242fe8c5a6d1ba2dd792cb16214'
  AND order_item_id = 1;

order_id,order_item_id,price,duplicate_status,_source_file_path,_ingestion_timestamp
00010242fe8c5a6d1ba2dd792cb16214,1,58.9,EXACT_DUPLICATE,/Volumes/dev_customer360/bronze/landing/olist/order_items/exact_duplicate_test_e71d908b5e984a4dbc34e0e8471d3356/part-00000-tid-5718681315376006654-8da28997-20bd-45b9-8653-900aa1abb141-1350-1-c000.csv,2026-10-10T12:04:57.255Z


In [0]:
%sql
SELECT
    COUNT(*) AS silver_record_count
FROM dev_customer360.silver.order_items
WHERE order_id = '00010242fe8c5a6d1ba2dd792cb16214'
  AND order_item_id = 1;

silver_record_count
1


In [0]:
%sql
SELECT
    (SELECT COUNT(*)
     FROM dev_customer360.bronze.bronze_order_items)
        AS bronze_rows,

    (SELECT COUNT(*)
     FROM dev_customer360.silver.order_items)
        AS silver_rows,

    (SELECT COUNT(*)
     FROM dev_customer360.silver.order_items_quarantine)
        AS quarantine_rows,

    (SELECT COUNT(*)
     FROM dev_customer360.silver.order_items_duplicates_audit)
        AS suppressed_duplicates;

bronze_rows,silver_rows,quarantine_rows,suppressed_duplicates
112652,112650,1,1


In [0]:
from pyspark.sql import functions as F

source_columns = [
    "order_id",
    "order_item_id",
    "product_id",
    "seller_id",
    "shipping_limit_date",
    "price",
    "freight_value"
]

conflict_source_df = (
    spark.table("dev_customer360.silver.order_items")
    .filter(
        (F.col("price") > 0) &
        (
            F.col("order_id") !=
            "00010242fe8c5a6d1ba2dd792cb16214"
        )
    )
    .orderBy("order_id", "order_item_id")
    .limit(1)
    .select(*source_columns)
)

display(conflict_source_df)

order_id,order_item_id,product_id,seller_id,shipping_limit_date,price,freight_value
00018f77f2f0320c557190d7a144bdd3,1,e5f2d52b802189ee658865ca93d83a8f,dd7ddc04e1b6c2c614352b383efe2d36,2017-05-03T11:05:13.000Z,239.90,19.93


In [0]:
%sql
SELECT
    'BRONZE' AS layer,
    COUNT(*) AS record_count
FROM dev_customer360.bronze.bronze_order_items
WHERE order_id = '00018f77f2f0320c557190d7a144bdd3'
  AND order_item_id = 1

UNION ALL

SELECT
    'SILVER',
    COUNT(*)
FROM dev_customer360.silver.order_items
WHERE order_id = '00018f77f2f0320c557190d7a144bdd3'
  AND order_item_id = 1

UNION ALL

SELECT
    'QUARANTINE',
    COUNT(*)
FROM dev_customer360.silver.order_items_quarantine
WHERE order_id = '00018f77f2f0320c557190d7a144bdd3'
  AND order_item_id = 1

UNION ALL

SELECT
    'DUPLICATE_AUDIT',
    COUNT(*)
FROM dev_customer360.silver.order_items_duplicates_audit
WHERE order_id = '00018f77f2f0320c557190d7a144bdd3'
  AND order_item_id = 1;

layer,record_count
BRONZE,1
SILVER,1
QUARANTINE,0
DUPLICATE_AUDIT,0


In [0]:
from pyspark.sql import functions as F
from uuid import uuid4

source_columns = [
    "order_id",
    "order_item_id",
    "product_id",
    "seller_id",
    "shipping_limit_date",
    "price",
    "freight_value"
]

# 1. Read the original business record
original_df = (
    spark.table("dev_customer360.bronze.bronze_order_items")
    .filter(
        (F.col("order_id") ==
         "00018f77f2f0320c557190d7a144bdd3") &
        (F.col("order_item_id") == 1)
    )
    .select(*source_columns)
)

# 2. Verify the baseline
assert original_df.count() == 1

original = original_df.first()

assert round(float(original["price"]), 2) == 239.90

# 3. Create a conflicting business version
conflict_df = (
    original_df
    .withColumn(
        "price",
        F.lit(289.90)
    )
)

assert conflict_df.count() == 1
assert round(float(conflict_df.first()["price"]), 2) == 289.90

# 4. Write a new CSV batch for Auto Loader
landing_path = (
    "/Volumes/dev_customer360/bronze/landing/"
    "olist/order_items"
)

output_path = (
    f"{landing_path}/"
    f"conflicting_duplicate_test_{uuid4().hex}"
)

(
    conflict_df
    .coalesce(1)
    .write
    .mode("append")
    .option("header", "true")
    .option(
        "timestampFormat",
        "yyyy-MM-dd'T'HH:mm:ss.SSSXXX"
    )
    .csv(output_path)
)

print("PASS: Conflicting duplicate CSV created")
print("Output path:", output_path)
print("Order ID:", original["order_id"])
print("Original price:", original["price"])
print("Conflicting price:", conflict_df.first()["price"])

PASS: Conflicting duplicate CSV created
Output path: /Volumes/dev_customer360/bronze/landing/olist/order_items/conflicting_duplicate_test_751a96905183471494b2a573e3b8a11a
Order ID: 00018f77f2f0320c557190d7a144bdd3
Original price: 239.9
Conflicting price: 289.9


In [0]:
%sql
WITH counts AS (
    SELECT
        (SELECT COUNT(*)
         FROM dev_customer360.bronze.bronze_order_items)
            AS bronze_rows,

        (SELECT COUNT(*)
         FROM dev_customer360.silver.order_items)
            AS silver_rows,

        (SELECT COUNT(*)
         FROM dev_customer360.silver.order_items_quarantine)
            AS quarantine_rows,

        (SELECT COUNT(*)
         FROM dev_customer360.silver.order_items_duplicates_audit)
            AS suppressed_duplicates
)

SELECT
    bronze_rows,
    silver_rows,
    quarantine_rows,
    suppressed_duplicates,
    silver_rows + quarantine_rows + suppressed_duplicates
        AS accounted_rows,
    bronze_rows - silver_rows - quarantine_rows
        - suppressed_duplicates AS reconciliation_difference
FROM counts;

bronze_rows,silver_rows,quarantine_rows,suppressed_duplicates,accounted_rows,reconciliation_difference
112653,112649,3,1,112653,0


In [0]:
%sql
SELECT
    order_id,
    order_item_id,
    price,
    duplicate_status,
    _dq_errors,
    _source_file_path
FROM dev_customer360.silver.order_items_quarantine
WHERE order_id = '00018f77f2f0320c557190d7a144bdd3'
  AND order_item_id = 1
ORDER BY price;

order_id,order_item_id,price,duplicate_status,_dq_errors,_source_file_path
00018f77f2f0320c557190d7a144bdd3,1,239.9,CONFLICTING_DUPLICATE,List(CONFLICTING_DUPLICATE),/Volumes/dev_customer360/bronze/landing/olist/order_items/olist_order_items_dataset.csv
00018f77f2f0320c557190d7a144bdd3,1,289.9,CONFLICTING_DUPLICATE,List(CONFLICTING_DUPLICATE),/Volumes/dev_customer360/bronze/landing/olist/order_items/conflicting_duplicate_test_751a96905183471494b2a573e3b8a11a/part-00000-tid-6847496961037619652-540443a0-1898-4cd3-91ec-1dd13185bc65-1378-1-c000.csv


In [0]:
%sql
SELECT COUNT(*) AS silver_record_count
FROM dev_customer360.silver.order_items
WHERE order_id = '00018f77f2f0320c557190d7a144bdd3'
  AND order_item_id = 1;

silver_record_count
0


In [0]:
%sql
SELECT
    COUNT(*) AS total_rows,
    COUNT(DISTINCT order_id) AS distinct_orders,

    COUNT(DISTINCT
        STRUCT(order_id, payment_sequential)
    ) AS distinct_payment_keys,

    SUM(CASE WHEN order_id IS NULL THEN 1 ELSE 0 END)
        AS null_order_ids,

    SUM(CASE WHEN payment_sequential IS NULL THEN 1 ELSE 0 END)
        AS null_payment_sequential,

    SUM(CASE WHEN payment_type IS NULL THEN 1 ELSE 0 END)
        AS null_payment_types,

    SUM(CASE WHEN payment_installments IS NULL THEN 1 ELSE 0 END)
        AS null_installments,

    SUM(CASE WHEN payment_value IS NULL THEN 1 ELSE 0 END)
        AS null_payment_values,

    SUM(CASE WHEN payment_value < 0 THEN 1 ELSE 0 END)
        AS negative_payment_values,

    SUM(CASE WHEN payment_value = 0 THEN 1 ELSE 0 END)
        AS zero_payment_values,

    SUM(CASE WHEN _rescued_data IS NOT NULL THEN 1 ELSE 0 END)
        AS rescued_rows

FROM dev_customer360.bronze.bronze_payments;

total_rows,distinct_orders,distinct_payment_keys,null_order_ids,null_payment_sequential,null_payment_types,null_installments,null_payment_values,negative_payment_values,zero_payment_values,rescued_rows
103886,99440,103886,0,0,0,0,0,0,9,0


In [0]:
%sql
SELECT
    payment_type,
    COUNT(*) AS total_payments,
    MIN(payment_value) AS min_payment,
    MAX(payment_value) AS max_payment,
    ROUND(AVG(payment_value), 2) AS avg_payment
FROM dev_customer360.bronze.bronze_payments
GROUP BY payment_type
ORDER BY total_payments DESC;

payment_type,total_payments,min_payment,max_payment,avg_payment
credit_card,76795,0.01,13664.08,163.32
boleto,19784,11.62,7274.88,145.03
voucher,5775,0.0,3184.34,65.7
debit_card,1529,13.38,4445.5,142.57
not_defined,3,0.0,0.0,0.0


In [0]:
spark.table(
    "dev_customer360.bronze.bronze_payments"
).printSchema()

root
 |-- order_id: string (nullable = true)
 |-- payment_sequential: integer (nullable = true)
 |-- payment_type: string (nullable = true)
 |-- payment_installments: integer (nullable = true)
 |-- payment_value: double (nullable = true)
 |-- _rescued_data: string (nullable = true)
 |-- _source_system: string (nullable = true)
 |-- _source_entity: string (nullable = true)
 |-- _source_file_path: string (nullable = true)
 |-- _source_file_name: string (nullable = true)
 |-- _source_file_size: long (nullable = true)
 |-- _source_file_modification_time: timestamp (nullable = true)
 |-- _ingestion_timestamp: timestamp (nullable = true)
 |-- _ingestion_date: date (nullable = true)
 |-- _record_hash: string (nullable = true)



In [0]:
%sql
SELECT
    payment_type,
    payment_installments,
    COUNT(*) AS total_records,
    SUM(
        CASE WHEN payment_value = 0 THEN 1 ELSE 0 END
    ) AS zero_value_records,
    SUM(
        CASE WHEN payment_installments <= 0 THEN 1 ELSE 0 END
    ) AS nonpositive_installments,
    MIN(payment_value) AS min_payment_value,
    MAX(payment_value) AS max_payment_value
FROM dev_customer360.bronze.bronze_payments
GROUP BY
    payment_type,
    payment_installments
ORDER BY
    payment_type,
    payment_installments;

payment_type,payment_installments,total_records,zero_value_records,nonpositive_installments,min_payment_value,max_payment_value
boleto,1,19784,0,0,11.62,7274.88
credit_card,0,2,0,2,58.69,129.94
credit_card,1,25455,0,0,0.01,13664.08
credit_card,2,12413,0,0,20.03,2442.82
credit_card,3,10461,0,0,30.0,3256.14
credit_card,4,7098,0,0,40.0,3126.5
credit_card,5,5239,0,0,49.99,4809.44
credit_card,6,3920,0,0,59.99,2828.42
credit_card,7,1626,0,0,69.97,2094.44
credit_card,8,4268,0,0,37.58,6929.31


In [0]:
%sql
SELECT
    order_id,
    payment_sequential,
    payment_type,
    payment_installments,
    payment_value
FROM dev_customer360.bronze.bronze_payments
WHERE payment_value = 0
   OR payment_installments <= 0
   OR payment_type = 'not_defined'
ORDER BY payment_type, order_id
LIMIT 50;

order_id,payment_sequential,payment_type,payment_installments,payment_value
1a57108394169c0b47d8f876acc9ba2d,2,credit_card,0,129.94
744bade1fcf9ff3f31d860ace076d422,2,credit_card,0,58.69
00b1cb0320190ca0daa2c88b35206009,1,not_defined,1,0.0
4637ca194b6387e2d538dc89b124b0ee,1,not_defined,1,0.0
c8c528189310eaa44a745b8d9d26908b,1,not_defined,1,0.0
45ed6e85398a87c253db47c2d9f48216,3,voucher,1,0.0
6ccb433e00daae1283ccc956189c82ae,4,voucher,1,0.0
8bcbe01d44d147f901cd3192671144db,4,voucher,1,0.0
b23878b3e8eb4d25a158f57d96331b18,4,voucher,1,0.0
fa65dad1b0e818e3ccc5cb0e39231352,13,voucher,1,0.0


In [0]:
%sql
WITH zero_payments AS (
    SELECT
        order_id,
        payment_sequential,
        payment_type,
        payment_installments,
        payment_value
    FROM dev_customer360.bronze.bronze_payments
    WHERE payment_value = 0
),
order_payment_summary AS (
    SELECT
        order_id,
        COUNT(*) AS payments_per_order,
        SUM(payment_value) AS total_order_payment,
        SUM(
            CASE WHEN payment_value > 0 THEN 1 ELSE 0 END
        ) AS positive_payment_count
    FROM dev_customer360.bronze.bronze_payments
    GROUP BY order_id
)
SELECT
    z.order_id,
    z.payment_sequential,
    z.payment_type,
    z.payment_value,
    s.payments_per_order,
    s.positive_payment_count,
    ROUND(s.total_order_payment, 2) AS total_order_payment
FROM zero_payments z
JOIN order_payment_summary s
    ON z.order_id = s.order_id
ORDER BY z.payment_type, z.order_id;

order_id,payment_sequential,payment_type,payment_value,payments_per_order,positive_payment_count,total_order_payment
00b1cb0320190ca0daa2c88b35206009,1,not_defined,0.0,1,0,0.0
4637ca194b6387e2d538dc89b124b0ee,1,not_defined,0.0,1,0,0.0
c8c528189310eaa44a745b8d9d26908b,1,not_defined,0.0,1,0,0.0
45ed6e85398a87c253db47c2d9f48216,3,voucher,0.0,3,2,71.14
6ccb433e00daae1283ccc956189c82ae,4,voucher,0.0,4,3,122.04
8bcbe01d44d147f901cd3192671144db,4,voucher,0.0,4,3,74.16
b23878b3e8eb4d25a158f57d96331b18,4,voucher,0.0,4,3,171.57
fa65dad1b0e818e3ccc5cb0e39231352,14,voucher,0.0,29,27,457.99
fa65dad1b0e818e3ccc5cb0e39231352,13,voucher,0.0,29,27,457.99


In [0]:
%sql
SELECT
    SUM(CASE WHEN order_id IS NULL THEN 1 ELSE 0 END)
        AS null_order_ids,

    SUM(CASE WHEN payment_sequential IS NULL
              OR payment_sequential <= 0
             THEN 1 ELSE 0 END)
        AS invalid_payment_sequence,

    SUM(CASE WHEN payment_type IS NULL THEN 1 ELSE 0 END)
        AS null_payment_types,

    SUM(CASE WHEN payment_installments IS NULL
             THEN 1 ELSE 0 END)
        AS null_installments,

    SUM(CASE WHEN payment_value IS NULL THEN 1 ELSE 0 END)
        AS null_payment_values,

    SUM(CASE WHEN payment_value < 0 THEN 1 ELSE 0 END)
        AS negative_payments,

    SUM(CASE WHEN _rescued_data IS NOT NULL THEN 1 ELSE 0 END)
        AS rescued_rows

FROM dev_customer360.bronze.bronze_payments;

null_order_ids,invalid_payment_sequence,null_payment_types,null_installments,null_payment_values,negative_payments,rescued_rows
0,0,0,0,0,0,0


In [0]:
spark.table(
    "dev_customer360.bronze.bronze_payments"
).printSchema()

root
 |-- order_id: string (nullable = true)
 |-- payment_sequential: integer (nullable = true)
 |-- payment_type: string (nullable = true)
 |-- payment_installments: integer (nullable = true)
 |-- payment_value: double (nullable = true)
 |-- _rescued_data: string (nullable = true)
 |-- _source_system: string (nullable = true)
 |-- _source_entity: string (nullable = true)
 |-- _source_file_path: string (nullable = true)
 |-- _source_file_name: string (nullable = true)
 |-- _source_file_size: long (nullable = true)
 |-- _source_file_modification_time: timestamp (nullable = true)
 |-- _ingestion_timestamp: timestamp (nullable = true)
 |-- _ingestion_date: date (nullable = true)
 |-- _record_hash: string (nullable = true)



In [0]:
%sql
SELECT 'BRONZE' AS layer, COUNT(*) AS records
FROM dev_customer360.bronze.bronze_payments

UNION ALL

SELECT 'SILVER', COUNT(*)
FROM dev_customer360.silver.payments

UNION ALL

SELECT 'QUARANTINE', COUNT(*)
FROM dev_customer360.silver.payments_quarantine;

layer,records
BRONZE,103886
SILVER,103881
QUARANTINE,5


In [0]:
%sql
SELECT 'Products' AS entity,
       (SELECT COUNT(*) FROM dev_customer360.bronze.bronze_products) AS bronze,
       COUNT(*) AS silver
FROM dev_customer360.silver.products

UNION ALL

SELECT 'Sellers',
       (SELECT COUNT(*) FROM dev_customer360.bronze.bronze_sellers),
       COUNT(*)
FROM dev_customer360.silver.sellers

UNION ALL

SELECT 'Reviews',
       (SELECT COUNT(*) FROM dev_customer360.bronze.bronze_reviews),
       COUNT(*)
FROM dev_customer360.silver.reviews

UNION ALL

SELECT 'Geolocation',
       (SELECT COUNT(*) FROM dev_customer360.bronze.bronze_geolocation),
       COUNT(*)
FROM dev_customer360.silver.geolocation

UNION ALL

SELECT 'Category Translation',
       (SELECT COUNT(*) FROM dev_customer360.bronze.bronze_category_translation),
       COUNT(*)
FROM dev_customer360.silver.category_translation;

entity,bronze,silver
Products,32951,32951
Sellers,3095,3095
Reviews,99224,99224
Geolocation,1000163,738332
Category Translation,71,71


In [0]:
%sql
SHOW TABLES IN dev_customer360.silver;

database,tableName,isTemporary
silver,category_translation,false
silver,customer_current,false
silver,customer_history,false
silver,geolocation,false
silver,order_current,false
silver,order_history,false
silver,order_items,false
silver,order_items_duplicates_audit,false
silver,order_items_quarantine,false
silver,payments,false


In [0]:
tables = [
    "customer_current",
    "order_current",
    "order_items",
    "payments",
    "reviews",
    "products",
    "sellers"
]

for table in tables:
    print(f"\n{'=' * 60}")
    print(f"TABLE: dev_customer360.silver.{table}")
    print("=" * 60)

    spark.table(
        f"dev_customer360.silver.{table}"
    ).printSchema()


TABLE: dev_customer360.silver.customer_current
root
 |-- customer_unique_id: string (nullable = true)
 |-- customer_id: string (nullable = true)
 |-- customer_zip_code_prefix: integer (nullable = true)
 |-- customer_city: string (nullable = true)
 |-- customer_state: string (nullable = true)
 |-- order_id: string (nullable = true)
 |-- order_purchase_timestamp: timestamp (nullable = true)
 |-- _event_timestamp: timestamp (nullable = true)
 |-- _change_id: string (nullable = true)
 |-- _rescued_data: string (nullable = true)
 |-- _source_system: string (nullable = true)
 |-- _source_entity: string (nullable = true)
 |-- _source_file_path: string (nullable = true)
 |-- _source_file_name: string (nullable = true)
 |-- _source_file_size: long (nullable = true)
 |-- _source_file_modification_time: timestamp (nullable = true)
 |-- _ingestion_timestamp: timestamp (nullable = true)
 |-- _ingestion_date: date (nullable = true)


TABLE: dev_customer360.silver.order_current
root
 |-- order_id: s

In [0]:
%sql
SELECT 'dim_customer_360' AS gold_table, COUNT(*) AS total_rows,
       COUNT(DISTINCT customer_unique_id) AS unique_keys
FROM dev_customer360.gold.dim_customer_360

UNION ALL

SELECT 'fact_orders', COUNT(*), COUNT(DISTINCT order_id)
FROM dev_customer360.gold.fact_orders

UNION ALL

SELECT 'fact_order_items', COUNT(*),
       COUNT(DISTINCT CONCAT_WS('|', order_id, CAST(order_item_id AS STRING)))
FROM dev_customer360.gold.fact_order_items

UNION ALL

SELECT 'customer_revenue_summary', COUNT(*),
       COUNT(DISTINCT customer_unique_id)
FROM dev_customer360.gold.customer_revenue_summary

UNION ALL

SELECT 'customer_rfm', COUNT(*),
       COUNT(DISTINCT customer_unique_id)
FROM dev_customer360.gold.customer_rfm;

gold_table,total_rows,unique_keys
dim_customer_360,96096,96096
fact_orders,99441,99441
fact_order_items,112649,112649
customer_revenue_summary,96096,96096
customer_rfm,96096,96096


In [0]:
%sql
SELECT
    (SELECT SUM(payment_value)
     FROM dev_customer360.silver.payments) AS silver_payments,

    (SELECT SUM(total_payment_value)
     FROM dev_customer360.gold.fact_orders) AS gold_payments;

silver_payments,gold_payments
16008683.49,16008683.49


In [0]:

from pyspark.sql import functions as F

# ==============================================
# Customer360 — Gold Validation
# ==============================================

CATALOG = "dev_customer360"

TABLES = {
    "customers": f"{CATALOG}.gold.dim_customer_360",
    "orders": f"{CATALOG}.gold.fact_orders",
    "order_items": f"{CATALOG}.gold.fact_order_items",
    "revenue": f"{CATALOG}.gold.customer_revenue_summary",
    "rfm": f"{CATALOG}.gold.customer_rfm",
    "mapping": f"{CATALOG}.gold.customer_order_mapping"
}

def check(condition, message):
    if not condition:
        raise ValueError(f"FAILED: {message}")
    print(f"PASSED: {message}")


# 1. Validate required tables and nonempty data

for name, table in TABLES.items():
    df = spark.table(table)
    count = df.count()

    check(count > 0, f"{name} contains records")
    print(f"{name}: {count:,} rows")


# 2. Validate business-key uniqueness

KEYS = {
    "customers": ["customer_unique_id"],
    "orders": ["order_id"],
    "order_items": ["order_id", "order_item_id"],
    "revenue": ["customer_unique_id"],
    "rfm": ["customer_unique_id"],
    "mapping": ["customer_id"]
}

for name, columns in KEYS.items():
    df = spark.table(TABLES[name])

    invalid_keys = df.filter(
        " OR ".join(
            f"`{column}` IS NULL"
            for column in columns
        )
    ).limit(1).count()

    check(invalid_keys == 0, f"{name}: no null keys")

    duplicates = (
        df.groupBy(*columns)
          .count()
          .filter(F.col("count") > 1)
          .limit(1)
          .count()
    )

    check(duplicates == 0, f"{name}: unique business keys")


# 3. Validate customer table relationships

customer_count = spark.table(TABLES["customers"]).count()
revenue_count = spark.table(TABLES["revenue"]).count()
rfm_count = spark.table(TABLES["rfm"]).count()

check(
    customer_count == revenue_count == rfm_count,
    "Customer, revenue and RFM counts match"
)


# 4. Validate payment reconciliation

silver_payments = spark.table(
    f"{CATALOG}.silver.payments"
)

gold_orders = spark.table(TABLES["orders"])

silver_total = silver_payments.agg(
    F.sum("payment_value").alias("total")
).first()["total"]

gold_total = gold_orders.agg(
    F.sum("total_payment_value").alias("total")
).first()["total"]

check(
    silver_total == gold_total,
    "Silver payments equal Gold order payments"
)

print(f"Silver payment total: {silver_total}")
print(f"Gold payment total:   {gold_total}")


# 5. Validate order-to-customer mapping coverage

unmapped_orders = (
    gold_orders.alias("o")
    .join(
        spark.table(TABLES["mapping"]).alias("m"),
        F.col("o.customer_id") == F.col("m.customer_id"),
        "left_anti"
    )
    .limit(1)
    .count()
)

check(
    unmapped_orders == 0,
    "Every Gold order has a customer mapping"
)


print("=" * 50)
print("CUSTOMER360 GOLD VALIDATION SUCCESSFUL")
print("=" * 50)


PASSED: customers contains records
customers: 96,096 rows
PASSED: orders contains records
orders: 99,441 rows
PASSED: order_items contains records
order_items: 112,649 rows
PASSED: revenue contains records
revenue: 96,096 rows
PASSED: rfm contains records
rfm: 96,096 rows
PASSED: mapping contains records
mapping: 99,446 rows
PASSED: customers: no null keys
PASSED: customers: unique business keys
PASSED: orders: no null keys
PASSED: orders: unique business keys
PASSED: order_items: no null keys
PASSED: order_items: unique business keys
PASSED: revenue: no null keys
PASSED: revenue: unique business keys
PASSED: rfm: no null keys
PASSED: rfm: unique business keys
PASSED: mapping: no null keys
PASSED: mapping: unique business keys
PASSED: Customer, revenue and RFM counts match
PASSED: Silver payments equal Gold order payments
Silver payment total: 16008683.49
Gold payment total:   16008683.49
PASSED: Every Gold order has a customer mapping
CUSTOMER360 GOLD VALIDATION SUCCESSFUL


In [0]:

# Find orders without matching customer mappings

unmapped = spark.sql("""
    SELECT
        o.order_id,
        o.customer_id,
        o.order_status,
        o.order_purchase_timestamp
    FROM dev_customer360.gold.fact_orders o
    LEFT ANTI JOIN
        dev_customer360.gold.customer_order_mapping m
    ON o.customer_id = m.customer_id
""")

print("Total unmapped orders:", unmapped.count())

display(unmapped.limit(20))


Total unmapped orders: 3345


order_id,customer_id,order_status,order_purchase_timestamp
00a250dbdb3153cc6ecf4d3f07ef6a17,ccff27cfcda46bdff5e51b6e6711a85c,delivered,2017-12-10T18:07:24.000Z
00c9d0257381c7e9ec13b4505f25b2cf,d14c86b99a98e85b5c256c081e3cea03,delivered,2018-04-18T08:57:18.000Z
00cee8a4dbb042385cbbd84699e78b2e,450a869eb52446baa38f4beeecbc5843,delivered,2018-07-20T04:13:54.000Z
01b37f50cf3098b3dd9d0450a188348c,d5161150c2e2a177eb4d49c4e2ab7990,delivered,2018-06-26T16:59:10.000Z
01dcbb39823b4cda39ddcc6679fb00ac,8e1dff0d67c90649dba1440b80328275,delivered,2017-05-29T20:01:57.000Z
02a0f7101947ebb4e6d2ec4c1c929bbb,2e2bf40d03d6ed228d47cf7fa49cf90b,delivered,2017-12-14T19:10:10.000Z
02c8875e5351540e76019fb7429e163f,7cbc9e8aed4560ebfd0195b5aa3be49c,delivered,2018-02-15T15:11:35.000Z
02c9b2b746777e4dadcf72941e5a010d,b9c7a79a20537b1e943044225f0b0113,delivered,2017-04-14T18:09:37.000Z
032de52b21013e176ee997c8f210dd66,dd810dd0a6c0af12c6450f51f139a2bf,delivered,2017-12-07T09:32:16.000Z
0362e923f805ae4dce58fd78c86c96c4,b49786f49847d2fecf5ba2d455321642,delivered,2018-04-13T13:54:38.000Z


In [0]:

from pyspark.sql import functions as F

orders = spark.table("dev_customer360.gold.fact_orders")
mapping = spark.table(
    "dev_customer360.gold.customer_order_mapping"
)

bronze = spark.table(
    "dev_customer360.bronze.bronze_customers"
)

unmapped = (
    orders.select("customer_id")
    .join(
        mapping.select("customer_id"),
        "customer_id",
        "left_anti"
    )
    .distinct()
)

bronze_ids = bronze.select("customer_id").distinct()

found_in_bronze = (
    unmapped.join(
        bronze_ids,
        "customer_id",
        "inner"
    )
    .count()
)

missing_in_bronze = (
    unmapped.join(
        bronze_ids,
        "customer_id",
        "left_anti"
    )
    .count()
)

print("Distinct unmapped customer IDs:", unmapped.count())
print("Found in Bronze:", found_in_bronze)
print("Missing in Bronze:", missing_in_bronze)


Distinct unmapped customer IDs: 3345
Found in Bronze: 3345
Missing in Bronze: 0


In [0]:

from pyspark.sql import functions as F

orders = spark.table(
    "dev_customer360.gold.fact_orders"
)

mapping = spark.table(
    "dev_customer360.gold.customer_order_mapping"
)

bronze = spark.table(
    "dev_customer360.bronze.bronze_customers"
)

current = spark.table(
    "dev_customer360.silver.customer_current"
)

# Customer IDs missing from the Gold mapping
unmapped = (
    orders.select("customer_id")
    .join(
        mapping.select("customer_id"),
        "customer_id",
        "left_anti"
    )
    .distinct()
)

# Check how many exist in the current-state table
found_in_current = (
    unmapped.join(
        current.select("customer_id").distinct(),
        "customer_id",
        "inner"
    )
    .count()
)

# Check whether the raw customer records have
# a valid customer_unique_id
bronze_matches = (
    unmapped.join(
        bronze.select(
            "customer_id",
            "customer_unique_id"
        ),
        "customer_id",
        "inner"
    )
)

missing_unique_id = (
    bronze_matches
    .filter(
        F.col("customer_unique_id").isNull()
        | (F.trim("customer_unique_id") == "")
    )
    .select("customer_id")
    .distinct()
    .count()
)

print("Unmapped customer IDs:", unmapped.count())
print("Found in Silver current:", found_in_current)
print("Missing unique ID in Bronze:", missing_unique_id)


Unmapped customer IDs: 3345
Found in Silver current: 0
Missing unique ID in Bronze: 0


In [0]:

from pyspark.sql import functions as F

orders = spark.table(
    "dev_customer360.gold.fact_orders"
)

mapping = spark.table(
    "dev_customer360.gold.customer_order_mapping"
)

# Identify orders without a customer mapping
unmapped_orders = (
    orders.alias("o")
    .join(
        mapping.alias("m"),
        F.col("o.customer_id") == F.col("m.customer_id"),
        "left_anti"
    )
    .count()
)

# Check mapping business-key uniqueness
duplicate_mapping_ids = (
    mapping.groupBy("customer_id")
    .count()
    .filter(F.col("count") > 1)
    .count()
)

print("Total Gold orders:", orders.count())
print("Total customer mappings:", mapping.count())
print("Unmapped orders:", unmapped_orders)
print("Duplicate mapping IDs:", duplicate_mapping_ids)

assert unmapped_orders == 0, "Customer mapping coverage failed"
assert duplicate_mapping_ids == 0, "Duplicate customer mappings found"

print("PASS: Customer mapping validation successful")


Total Gold orders: 99441
Total customer mappings: 99446
Unmapped orders: 0
Duplicate mapping IDs: 0
PASS: Customer mapping validation successful


In [0]:
%sql

SHOW TABLES IN dev_customer360.silver;


database,tableName,isTemporary
silver,category_translation,false
silver,customer_current,false
silver,customer_history,false
silver,geolocation,false
silver,order_current,false
silver,order_history,false
silver,order_items,false
silver,order_items_duplicates_audit,false
silver,order_items_quarantine,false
silver,payments,false


In [0]:
%sql
DESCRIBE TABLE dev_customer360.silver.customer_history;


col_name,data_type,comment
customer_unique_id,string,null
customer_id,string,null
customer_zip_code_prefix,int,null
customer_city,string,null
customer_state,string,null
order_id,string,null
order_purchase_timestamp,timestamp,null
_event_timestamp,timestamp,null
_change_id,string,null
__START_AT,int,null


In [0]:
%sql
DESCRIBE TABLE dev_customer360.silver.customer_current;

col_name,data_type,comment
customer_unique_id,string,null
customer_id,string,null
customer_zip_code_prefix,int,null
customer_city,string,null
customer_state,string,null
order_id,string,null
order_purchase_timestamp,timestamp,null
_event_timestamp,timestamp,null
_change_id,string,null
_rescued_data,string,null


In [0]:
%sql
WITH history_checks AS (
    SELECT
        customer_unique_id,
        COUNT(*) AS total_versions,

        SUM(
            CASE
                WHEN __END_AT IS NULL THEN 1
                ELSE 0
            END
        ) AS active_versions,

        SUM(
            CASE
                WHEN __END_AT IS NOT NULL
                 AND __END_AT <= __START_AT
                THEN 1
                ELSE 0
            END
        ) AS invalid_boundaries,

        COUNT(DISTINCT __START_AT) AS distinct_starts

    FROM dev_customer360.silver.customer_history
    GROUP BY customer_unique_id
)

SELECT
    COUNT(*) AS total_customers,

    SUM(
        CASE WHEN active_versions > 1 THEN 1 ELSE 0 END
    ) AS multiple_active_customers,

    SUM(
        CASE WHEN invalid_boundaries > 0 THEN 1 ELSE 0 END
    ) AS customers_with_invalid_boundaries,

    SUM(
        CASE WHEN distinct_starts <> total_versions THEN 1 ELSE 0 END
    ) AS customers_with_duplicate_start_sequences,

    SUM(
        CASE WHEN total_versions > 1 THEN 1 ELSE 0 END
    ) AS customers_with_history

FROM history_checks;


total_customers,multiple_active_customers,customers_with_invalid_boundaries,customers_with_duplicate_start_sequences,customers_with_history
96097,0,0,0,253


In [0]:
%sql

WITH active_history AS (
    SELECT
        customer_unique_id
    FROM dev_customer360.silver.customer_history
    WHERE __END_AT IS NULL
),

current_customers AS (
    SELECT
        customer_unique_id
    FROM dev_customer360.silver.customer_current
)

SELECT
    (SELECT COUNT(*) FROM active_history)
        AS active_history_rows,

    (SELECT COUNT(*) FROM current_customers)
        AS current_customer_rows,

    (
        SELECT COUNT(*)
        FROM active_history h
        LEFT ANTI JOIN current_customers c
            ON h.customer_unique_id = c.customer_unique_id
    ) AS missing_from_current,

    (
        SELECT COUNT(*)
        FROM current_customers c
        LEFT ANTI JOIN active_history h
            ON c.customer_unique_id = h.customer_unique_id
    ) AS missing_from_history;


active_history_rows,current_customer_rows,missing_from_current,missing_from_history
96096,96096,0,0


In [0]:
%sql

SELECT
    customer_unique_id,
    COUNT(*) AS total_versions,
    MIN(__START_AT) AS first_sequence,
    MAX(__END_AT) AS last_end_sequence
FROM dev_customer360.silver.customer_history
GROUP BY customer_unique_id
HAVING SUM(
    CASE
        WHEN __END_AT IS NULL THEN 1
        ELSE 0
    END
) = 0;


customer_unique_id,total_versions,first_sequence,last_end_sequence
SIM_CUST_UNIQUE_001,1,1,2


In [0]:
%sql
DESCRIBE TABLE dev_customer360.silver.order_current;


col_name,data_type,comment
order_id,string,null
customer_id,string,null
order_status,string,null
order_purchase_timestamp,timestamp,null
order_approved_at,timestamp,null
order_delivered_carrier_date,timestamp,null
order_delivered_customer_date,timestamp,null
order_estimated_delivery_date,timestamp,null
_event_type,string,null
_lifecycle_rank,int,null


In [0]:
%sql
DESCRIBE TABLE dev_customer360.silver.order_history;


col_name,data_type,comment
order_id,string,null
customer_id,string,null
order_status,string,null
order_purchase_timestamp,timestamp,null
order_approved_at,timestamp,null
order_delivered_carrier_date,timestamp,null
order_delivered_customer_date,timestamp,null
order_estimated_delivery_date,timestamp,null
_event_type,string,null
_lifecycle_rank,int,null


In [0]:
%sql

WITH order_checks AS (
    SELECT
        order_id,
        COUNT(*) AS total_versions,

        SUM(
            CASE
                WHEN __END_AT IS NULL THEN 1
                ELSE 0
            END
        ) AS active_versions,

        SUM(
            CASE
                WHEN __END_AT IS NOT NULL
                 AND __END_AT <= __START_AT
                THEN 1
                ELSE 0
            END
        ) AS invalid_boundaries,

        COUNT(DISTINCT __START_AT)
            AS distinct_start_sequences

    FROM dev_customer360.silver.order_history
    GROUP BY order_id
)

SELECT
    COUNT(*) AS total_orders,

    SUM(
        CASE
            WHEN active_versions > 1 THEN 1
            ELSE 0
        END
    ) AS orders_with_multiple_active_versions,

    SUM(
        CASE
            WHEN invalid_boundaries > 0 THEN 1
            ELSE 0
        END
    ) AS orders_with_invalid_boundaries,

    SUM(
        CASE
            WHEN distinct_start_sequences <> total_versions
            THEN 1
            ELSE 0
        END
    ) AS orders_with_duplicate_start_sequences,

    SUM(
        CASE
            WHEN total_versions > 1 THEN 1
            ELSE 0
        END
    ) AS orders_with_history,

    SUM(
        CASE
            WHEN active_versions = 0 THEN 1
            ELSE 0
        END
    ) AS orders_without_active_version

FROM order_checks;


total_orders,orders_with_multiple_active_versions,orders_with_invalid_boundaries,orders_with_duplicate_start_sequences,orders_with_history,orders_without_active_version
99442,0,0,0,99295,1


In [0]:
%sql
WITH active_history AS (
    SELECT
        order_id,
        order_status,
        _lifecycle_rank
    FROM dev_customer360.silver.order_history
    WHERE __END_AT IS NULL
),

current_orders AS (
    SELECT
        order_id,
        order_status,
        _lifecycle_rank
    FROM dev_customer360.silver.order_current
)

SELECT
    (SELECT COUNT(*) FROM active_history)
        AS active_history_rows,

    (SELECT COUNT(*) FROM current_orders)
        AS current_order_rows,

    (
        SELECT COUNT(*)
        FROM active_history h
        LEFT ANTI JOIN current_orders c
            ON h.order_id = c.order_id
    ) AS missing_from_current,

    (
        SELECT COUNT(*)
        FROM current_orders c
        LEFT ANTI JOIN active_history h
            ON c.order_id = h.order_id
    ) AS missing_from_history,

    (
        SELECT COUNT(*)
        FROM active_history h
        INNER JOIN current_orders c
            ON h.order_id = c.order_id
        WHERE NOT (
            h.order_status <=> c.order_status
            AND h._lifecycle_rank <=> c._lifecycle_rank
        )
    ) AS mismatched_order_states;


active_history_rows,current_order_rows,missing_from_current,missing_from_history,mismatched_order_states
99441,99441,0,0,0


In [0]:
%sql

SELECT
    order_id,
    COUNT(*) AS total_versions,
    MIN(__START_AT) AS first_sequence,
    MAX(__END_AT) AS last_end_sequence,
    MAX(_lifecycle_rank) AS maximum_lifecycle_rank
FROM dev_customer360.silver.order_history
GROUP BY order_id
HAVING SUM(
    CASE
        WHEN __END_AT IS NULL THEN 1
        ELSE 0
    END
) = 0;


order_id,total_versions,first_sequence,last_end_sequence,maximum_lifecycle_rank
SIM_ORDER_DELETE_TEST_001,1,1,2,1


In [0]:
%sql

SELECT 'customer_current' AS table_name,
       COUNT(*) AS row_count
FROM dev_customer360.silver.customer_current

UNION ALL

SELECT 'customer_history',
       COUNT(*)
FROM dev_customer360.silver.customer_history

UNION ALL

SELECT 'order_current',
       COUNT(*)
FROM dev_customer360.silver.order_current

UNION ALL

SELECT 'order_history',
       COUNT(*)
FROM dev_customer360.silver.order_history

UNION ALL

SELECT 'fact_orders',
       COUNT(*)
FROM dev_customer360.gold.fact_orders

UNION ALL

SELECT 'fact_order_items',
       COUNT(*)
FROM dev_customer360.gold.fact_order_items

ORDER BY table_name;


table_name,row_count
customer_current,96096
customer_history,96358
fact_order_items,112649
fact_orders,99441
order_current,99441
order_history,392694


In [0]:
%sql

SELECT 'customer_current' AS table_name,
       COUNT(*) AS row_count
FROM dev_customer360.silver.customer_current

UNION ALL

SELECT 'customer_history', COUNT(*)
FROM dev_customer360.silver.customer_history

UNION ALL

SELECT 'order_current', COUNT(*)
FROM dev_customer360.silver.order_current

UNION ALL

SELECT 'order_history', COUNT(*)
FROM dev_customer360.silver.order_history

UNION ALL

SELECT 'fact_orders', COUNT(*)
FROM dev_customer360.gold.fact_orders

UNION ALL

SELECT 'fact_order_items', COUNT(*)
FROM dev_customer360.gold.fact_order_items

ORDER BY table_name;


table_name,row_count
customer_current,96096
customer_history,96358
fact_order_items,112649
fact_orders,99441
order_current,99441
order_history,392694


In [0]:
%sql

WITH duplicate_checks AS (

    SELECT
        'customer_current' AS table_name,
        COUNT(*) - COUNT(DISTINCT customer_unique_id)
            AS duplicate_count
    FROM dev_customer360.silver.customer_current

    UNION ALL

    SELECT
        'customer_history',
        COUNT(*) - COUNT(DISTINCT
            customer_unique_id, __START_AT
        )
    FROM dev_customer360.silver.customer_history

    UNION ALL

    SELECT
        'order_current',
        COUNT(*) - COUNT(DISTINCT order_id)
    FROM dev_customer360.silver.order_current

    UNION ALL

    SELECT
        'order_history',
        COUNT(*) - COUNT(DISTINCT
            order_id, __START_AT
        )
    FROM dev_customer360.silver.order_history

    UNION ALL

    SELECT
        'fact_orders',
        COUNT(*) - COUNT(DISTINCT order_id)
    FROM dev_customer360.gold.fact_orders
)

SELECT
    table_name,
    duplicate_count,
    CASE
        WHEN duplicate_count = 0 THEN 'PASS'
        ELSE 'FAIL'
    END AS validation_status
FROM duplicate_checks
ORDER BY table_name;


table_name,duplicate_count,validation_status
customer_current,0,PASS
customer_history,0,PASS
fact_orders,0,PASS
order_current,0,PASS
order_history,0,PASS


In [0]:
%sql

SELECT
    'silver_order_items' AS layer,
    COUNT(*) AS total_rows,
    COUNT(DISTINCT order_id) AS distinct_orders
FROM dev_customer360.silver.order_items

UNION ALL

SELECT
    'gold_fact_order_items',
    COUNT(*),
    COUNT(DISTINCT order_id)
FROM dev_customer360.gold.fact_order_items;


layer,total_rows,distinct_orders
silver_order_items,112649,98665
gold_fact_order_items,112649,98665


In [0]:
%sql

DESCRIBE TABLE dev_customer360.gold.fact_order_items;


col_name,data_type,comment
order_id,string,null
order_item_id,int,null
product_id,string,null
seller_id,string,null
product_category,string,null
product_category_english,string,null
seller_city,string,null
seller_state,string,null
shipping_limit_date,timestamp,null
item_price,"decimal(18,2)",null


In [0]:
%sql
WITH silver_keys AS (
    SELECT
        order_id,
        order_item_id
    FROM dev_customer360.silver.order_items
),

gold_keys AS (
    SELECT
        order_id,
        order_item_id
    FROM dev_customer360.gold.fact_order_items
),

missing_in_gold AS (
    SELECT order_id, order_item_id
    FROM silver_keys

    EXCEPT ALL

    SELECT order_id, order_item_id
    FROM gold_keys
),

extra_in_gold AS (
    SELECT order_id, order_item_id
    FROM gold_keys

    EXCEPT ALL

    SELECT order_id, order_item_id
    FROM silver_keys
)

SELECT
    (SELECT COUNT(*) FROM missing_in_gold)
        AS missing_in_gold,

    (SELECT COUNT(*) FROM extra_in_gold)
        AS extra_in_gold,

    CASE
        WHEN (SELECT COUNT(*) FROM missing_in_gold) = 0
         AND (SELECT COUNT(*) FROM extra_in_gold) = 0
        THEN 'PASS'
        ELSE 'FAIL'
    END AS reconciliation_status;


missing_in_gold,extra_in_gold,reconciliation_status
0,0,PASS


In [0]:
%sql

WITH silver_totals AS (
    SELECT
        COUNT(*) AS total_rows,
        ROUND(SUM(price), 2) AS total_item_price,
        ROUND(SUM(freight_value), 2) AS total_freight,
        ROUND(SUM(price + freight_value), 2)
            AS total_order_item_value
    FROM dev_customer360.silver.order_items
),

gold_totals AS (
    SELECT
        COUNT(*) AS total_rows,
        ROUND(SUM(item_price), 2) AS total_item_price,
        ROUND(SUM(freight_value), 2) AS total_freight,
        ROUND(SUM(item_total_value), 2)
            AS total_order_item_value
    FROM dev_customer360.gold.fact_order_items
)

SELECT
    s.total_rows AS silver_rows,
    g.total_rows AS gold_rows,

    s.total_item_price AS silver_item_price,
    g.total_item_price AS gold_item_price,

    s.total_freight AS silver_freight,
    g.total_freight AS gold_freight,

    s.total_order_item_value AS silver_total_value,
    g.total_order_item_value AS gold_total_value,

    CASE
        WHEN s.total_rows = g.total_rows
         AND s.total_item_price <=> g.total_item_price
         AND s.total_freight <=> g.total_freight
         AND s.total_order_item_value <=> g.total_order_item_value
        THEN 'PASS'
        ELSE 'FAIL'
    END AS reconciliation_status

FROM silver_totals s
CROSS JOIN gold_totals g;


silver_rows,gold_rows,silver_item_price,gold_item_price,silver_freight,gold_freight,silver_total_value,gold_total_value,reconciliation_status
112649,112649,13591403.80,13591403.80,2251889.61,2251889.61,15843293.41,15843293.41,PASS


In [0]:
%sql

WITH item_comparison AS (
    SELECT
        s.order_id,
        s.order_item_id,
        s.price AS silver_price,
        g.item_price AS gold_price,
        s.freight_value AS silver_freight,
        g.freight_value AS gold_freight,
        g.item_total_value AS gold_total
    FROM dev_customer360.silver.order_items s
    INNER JOIN dev_customer360.gold.fact_order_items g
        ON s.order_id = g.order_id
       AND s.order_item_id = g.order_item_id
)

SELECT
    COUNT(*) AS compared_rows,

    SUM(
        CASE
            WHEN NOT (
                CAST(silver_price AS DECIMAL(18,2))
                <=> gold_price
            )
            THEN 1 ELSE 0
        END
    ) AS price_mismatches,

    SUM(
        CASE
            WHEN NOT (
                CAST(silver_freight AS DECIMAL(18,2))
                <=> gold_freight
            )
            THEN 1 ELSE 0
        END
    ) AS freight_mismatches,

    SUM(
        CASE
            WHEN NOT (
                CAST(
                    silver_price + silver_freight
                    AS DECIMAL(19,2)
                ) <=> gold_total
            )
            THEN 1 ELSE 0
        END
    ) AS total_value_mismatches

FROM item_comparison;


compared_rows,price_mismatches,freight_mismatches,total_value_mismatches
112649,0,0,0
